## ISSCC 2026 Code-a-Chip Challenge

## A Python-Based Semi-Automatic Layout Generation Flow for Current Ouputs Design in an Open-Source Environment

Onchip Team, November 2025 \
SPDX-License-Identifier: Apache-2.0

|Name|Affiliation|IEEE Member|SSCS Member|Email|
|:--:|:----------:|:----------:|:----------:|:----------:|
|Sebastian Suarez Velazco|Universidad Industrial de Santander (UIS) |Yes|Yes|sebastian.suarez.velazco@gmail.com|
|Jose Felix Algarín Cotes|Universidad Industrial de Santander (UIS) |No|No|josefelixac21@gmail.com|
|Julian Romero|Universidad Industrial de Santander (UIS) |No|No|julian03160022@gmail.com|
|Ramón Stiven Sarmiento|Universidad Industrial de Santander (UIS) |No|No|ramon2200503@correo.uis.edu.co|
|Alex Mantilla|Universidad Industrial de Santander (UIS) |Yes|Yes|alexmantilla97@gmail.com|
|Javier Ardila|Universidad Industrial de Santander (UIS) |Yes|Yes|jardilao@uis.edu.co|
---
# Introduction
The layout design of analog integrated circuits remains one of the most demanding stages in the design flow. Generating a layout that satisfies design rule checks (DRC) and layout versus schematic (LVS) verification is time-consuming when performed manually. Recent approaches aiming for full automation, including large language models and reinforcement learning-based optimizers. Although these approaches are promising and aim for full automation, they rely on complex models that require substantial computational resources, limiting their practical applicability.

This Noteboook propose an intermediate approach that combines designer interaction with a semi-automatic layout generation flow, implemented in Python on top of the open-source [GLayout framework](https://github.com/ReaLLMASIC/gLayout). The methodology reduces layout design time by structured configuration inputs, such as matrices that define transistor placement, along with dictionaries that describe device parameters. This approach optimizes a key stage of the design flow while relying solely on open-source tools and minimal computational resources. The proposed methodology is validated through current output circuit, implemented in the GF180 PDK, demonstrating adaptability to different design objectives. This work implements the complete flow through the open-source container [IIC-OSIC-TOOLS](https://github.com/iic-jku/IIC-OSIC-TOOLS), which integrates all the necessary tools for every design step, ensuring consistency across design stages and enabling advanced analyses.

---
# Set-up the enviroment


In [1]:
#@title Imports
from glayout import MappedPDK, sky130, gf180
from glayout import nmos, pmos, tapring, via_stack, via_array
from glayout.primitives.fet import __gen_fingers_macro

from glayout.spice.netlist import Netlist
from glayout.routing import c_route, L_route, straight_route

from gdsfactory.cell import cell
from gdsfactory.component import Component, copy
from gdsfactory.components.rectangle import rectangle
from gdsfactory.routing.route_quad import route_quad
from gdsfactory.routing.route_sharp import route_sharp

from glayout.util.comp_utils import (
    align_comp_to_port,
    evaluate_bbox,
    movex,
    movey,
    prec_ref_center,
    prec_array,
)
from glayout.util.port_utils import (
    add_ports_perimeter,
    get_orientation,
    print_ports,
    rename_ports_by_list,
    rename_ports_by_orientation,
    set_port_orientation,
)
from glayout.util.snap_to_grid import component_snap_to_grid
from glayout.placement.common_centroid_ab_ba import common_centroid_ab_ba

from gdsfactory.functions import transformed
from gdsfactory.components import text_freetype
from gdsfactory.components.rectangular_ring import rectangular_ring
from typing import Optional, Union, Literal
import time
import copy
import gdsfactory as gf

# Numerical functions
from decimal import Decimal

import IPython.display
from IPython.display import clear_output
import gdstk
import svgutils.transform as sg
import ipywidgets as widgets


In [2]:
# Redirect all outputs here
hide = widgets.Output()

def display_gds(gds_file, name, scale = 3):
  # Generate an SVG image
  top_level_cell = gdstk.read_gds(gds_file).top_level()[0]
  top_level_cell.write_svg(f'{name}.svg')
  # Scale the image for displaying
  fig = sg.fromfile(f'{name}.svg')
  fig.set_size((str(float(fig.width) * scale), str(float(fig.height) * scale)))
  fig.save(f'{name}.svg')

  # Display the image
  IPython.display.display(IPython.display.SVG(f'{name}.svg'))

def display_component(component, name, scale = 3):
  # Save to a GDS file
  with hide:
    component.write_gds(f"{name}.gds")
  display_gds(f'{name}.gds', name, scale)

The function macro_two_transistor_placement_Onchip implements a parametric layout generator for two-transistor arrays (devices A and B), compatible with the [SkyWater SKY130](https://skywater-pdk.readthedocs.io/en/main/index.html) and [GF180 PDKs](https://gf180mcu-pdk.readthedocs.io/en/latest/index.html). Its output is an object representing the complete transistor placement, including dummy devices, well and substrate rings, internal interconnection routes, and external ports intended for integration with subsequent circuit design stages.

For proper operation, the function requires as input the mapped PDK (pdk), the transistor type to instantiate for both devices (deviceA_and_B, either "nfet" or "pfet"), the geometrical parameters of the device (width width1, channel length length1, and number of fingers fingers1), and a scaling factor for metal route widths (width_route_mult).

The spatial arrangement of the devices is defined by the matrix matriz, where each entry specifies the element placed in that cell: 1 corresponds to transistor A, 2 to transistor B, and 0 to a dummy device. Optionally, the layout can include dummy transistors (with_dummy) around the active devices, additional substrate contacts for PFETs (with_substrate_tap), and a tie ring connecting the bulk/well to metal (with_tie). Furthermore, the parameter with_lvt_layer enables the inclusion of a Low-Voltage Threshold (LVT) layer associated with the taps, while full_output_size allows the export of additional ports, facilitating integration with higher-level routing and hierarchical layout generation.

In [3]:
def macro_two_transistor_placement_Onchip(
    pdk: MappedPDK,
    deviceA_and_B: Literal["nfet", "pfet"],
    width_route_mult: float = 1,
    with_substrate_tap: bool = False,
    with_tie: bool = True,
    width1: float = 1,
    length1: float = 2,
    fingers1: int = 1,
    matriz: list = [[1, 2, 1], [2, 1, 2]],
    with_dummy: bool = False,
    with_lvt_layer: bool = True,
    full_output_size: bool = False,
    **kwargs,
) -> Component:
    # This code was made by Sebastian Suarez y Jose Algarin, UIS Electronic engineering students
    """Two transistors Placement generator
    args:
    pdk = pdk to use
    deviceA_and_B = the device to place for both transistors (either nfet or pfet)
    width_route_mult = thickness of metal routes escaled (int only)
    with_substrate_tap = add substrate tap
    with_tie = Add Bulk connections
    width1 = transistor width
    length1 = transitor length
    fingers1 = introduces additional fingers to transistor (sharing s/d)
    matriz = Devices array for placement
    with_dummy =  Add dummys around placement
    with_lvt_layer = add lvt layer
    full_output_size = save the full position of the ports for the power_rails_placement function (A_source_T_, B_source_T_, A_drain_T_, B_drain_T_)

    ports (one port for each edge),
    ****NOTE: source is below drain:
    A_source_... all edges (met3 vertical met4 horizontal)
    B_source_... all edges (met3 vertical met4 horizontal)
    A_gate_... all edges (met3 vertical met4 horizontal)
    B_gate_... all edges (met3 vertical met4 horizontal)
    A_drain_... all edges (met3 vertical met4 horizontal)
    B_drain_... all edges (met3 vertical met4 horizontal)
    bulk_... all edges (met3 vertical met4 horizontal)
    """
    pdk_gf180 = False
    pdk_sky130 = True
    if pdk is gf180:
        pdk_gf180 = True
        pdk_sky130 = False
    elif pdk is sky130:
        pdk_gf180 = False
        pdk_sky130 = True

    if width_route_mult > 5 or width_route_mult < 0:
        raise ValueError("width_route is out of range")

    matplace = Component()
    matriz = copy.deepcopy(matriz)
    enable_B = False
    for fila in matriz:
        for transistor in fila:
            if transistor == 2:
                enable_B = True
                break
    # Add dummys to array (matriz)
    if with_dummy:
        len_matriz_with_dumys = len(matriz[0]) + 2
        for row in matriz:
            row.insert(0, 0)
            row.append(0)
        matriz.insert(0, [0] * len_matriz_with_dumys)
        matriz.insert(len(matriz), [0] * len_matriz_with_dumys)
    # Check if rows are are odd or even
    if (len(matriz)) % 2 == 0:
        middle_transistor = len(matriz) // 2
        even = True
    else:
        even = False
    matrizT = [list(fila) for fila in zip(*matriz)]
    # Overwrite kwargs for needed options
    kwargs["sdlayer"] = "n+s/d" if deviceA_and_B == "nfet" else "p+s/d"
    kwargs["pdk"] = pdk
    kwargs["dummy"] = (False, False)
    # Insert modifications for dummies
    kwargs["routing"] = False
    kwargs["gate_route_extension"] = pdk.snap_to_2xgrid(0)
    if with_dummy:
        dummy_single_down = multiplier(
            width=width1, length=length1, fingers=1, gate_down=True, **kwargs
        )
        dummy_single_up = multiplier(
            width=width1, length=length1, fingers=1, gate_up=True, **kwargs
        )
        devDT = multiplier(
            width=width1, length=length1, fingers=fingers1, gate_up=True, **kwargs
        )
        devDB = multiplier(
            width=width1, length=length1, fingers=fingers1, gate_down=True, **kwargs
        )
    # Insert modifications for device A
    kwargs["routing"] = True
    devA_gate_extension = (
        abs(pdk.get_grule("met2")["min_separation"] + devDT.ports["gate_W"].width)
        if with_dummy
        else abs(pdk.get_grule("met2")["min_separation"])
    )
    devA_sd_extension = abs(pdk.get_grule("met2")["min_separation"])
    kwargs["gate_route_extension"] = pdk.snap_to_2xgrid(devA_gate_extension)
    kwargs["sd_route_extension"] = pdk.snap_to_2xgrid(devA_sd_extension+0.1)
    devA = multiplier(
        width=width1, length=length1, fingers=fingers1, rmult=width_route_mult, **kwargs
    )
    # Insert kwarg modfications for device B
    devB_sd_extension = abs(
        devA.ports["drain_N"].center[1] - devA.ports["diff_N"].center[1]
    )
    devB_gate_extension = (
        abs(2 * (pdk.get_grule("met2")["min_separation"] + devA.ports["gate_W"].width))
        if with_dummy
        else abs(
            2 * pdk.get_grule("met2")["min_separation"] + devA.ports["gate_W"].width
        )
    )
    kwargs["sd_route_extension"] = pdk.snap_to_2xgrid(devB_sd_extension+0.1)
    kwargs["gate_route_extension"] = pdk.snap_to_2xgrid(devB_gate_extension)
    devB = multiplier(
        width=width1, length=length1, fingers=fingers1, rmult=width_route_mult, **kwargs
    )
    # Create the array of transistors
    transistors = list()
    for i in range(len(matriz)):
        transistors_in_row = list()
        for j in range(len(matriz[i])):
            if i == 0 or i == len(matriz) - 1:  # first and last row
                if j == 0 or j == len(matriz[i]) - 1:  # first and last column
                    # corner transistors
                    if matriz[i][j] == 0 and i == 0:
                        # small dummy
                        transistors_in_row.append(matplace << dummy_single_down)
                    elif matriz[i][j] == 0 and i == len(matriz) - 1:
                        # small dummy
                        transistors_in_row.append(matplace << dummy_single_up)
                    else:
                        if matriz[i][j] == 1:
                            transistors_in_row.append(matplace << devA)
                        elif matriz[i][j] == 2:
                            transistors_in_row.append(matplace << devB)
                elif i == 0:  # first row
                    # first row transistors
                    if matriz[i][j] == 0:
                        # dummy
                        transistors_in_row.append(matplace << devDB)
                    else:
                        if matriz[i][j] == 1:
                            transistors_in_row.append(matplace << devA)
                        elif matriz[i][j] == 2:
                            transistors_in_row.append(matplace << devB)
                else:  # last row
                    # last row transistors
                    if matriz[i][j] == 0:
                        # dummy
                        transistors_in_row.append(matplace << devDT)
                    else:
                        if matriz[i][j] == 1:
                            transistors_in_row.append(matplace << devA)
                        elif matriz[i][j] == 2:
                            transistors_in_row.append(matplace << devB)
            else:  # middle rows
                if matriz[i][j] == 0:
                    # small dummy
                    transistors_in_row.append(matplace << dummy_single_down)
                else:
                    if matriz[i][j] == 1:
                        transistors_in_row.append(matplace << devA)
                    elif matriz[i][j] == 2:
                        transistors_in_row.append(matplace << devB)

        # Add the transistors in the row
        transistors.append(transistors_in_row)
    # min separation
    min_separation_x = pdk.snap_to_2xgrid(pdk.get_grule("p+s/d")["min_separation"])
    if pdk == sky130:
        min_separation = pdk.get_grule("poly")["min_separation"]
    elif pdk == gf180:
        min_separation = pdk.get_grule("met2")["min_separation"]
    for i in range(len(transistors)):
        # Move the transistors in y direction
        if i == 0:
            # first row dont move
            ymove = 0
        else:  # find max y size in the row
            distance_center2bottom_ref = transistors[i][0].bbox[0][1]  # Temporal
            distance_center2top_pre_ref = (
                transistors[i - 1][0].bbox[1][1] - ymove
            )  # Temporal // Minus the ymove because this one was already moved
            for k in range(len(transistors[i])):
                distance_center2bottom_temp = transistors[i][k].bbox[0][
                    1
                ]  # distance center to bottom of the transistor that will be moved
                distance_center2top_pre_temp = (
                    transistors[i - 1][k].bbox[1][1] - ymove
                )  # distance center to top of the transistor above the one that will be moved
                if (
                    distance_center2bottom_temp < distance_center2bottom_ref
                ):  # minus because the distance is negative
                    distance_center2bottom_ref = distance_center2bottom_temp
                if distance_center2top_pre_temp > distance_center2top_pre_ref:
                    distance_center2top_pre_ref = distance_center2top_pre_temp

            ymove_temp = (
                abs(distance_center2bottom_ref)
                + abs(distance_center2top_pre_ref)
                + min_separation +0.01
            )
            ymove += ymove_temp
            if even and i == middle_transistor:
                # If even need more space in the middle row for the output
                extra_space = pdk.snap_to_2xgrid(
                    evaluate_bbox(via_stack(pdk, "met2", "met3"))[1]
                    + 2 * pdk.get_grule("met2")["min_separation"] + 0.01
                )
                ymove += extra_space
        for j in range(len(transistors[i])):
            size_transistor = evaluate_bbox(transistors[i][j])
            # Move the transistors in x direction
            if j == 0:
                # first transistor dont move
                xmove = 0
            else:
                pre_last_size = evaluate_bbox(transistors[i][j - 1])
                # rest of transistors
                xmove += (size_transistor[0] + pre_last_size[0]) / 2 + min_separation_x +0.01
            transistors[i][j].movex(pdk.snap_to_2xgrid(xmove))
            transistors[i][j].movey(pdk.snap_to_2xgrid(ymove))
            if matriz[i][j] == 0:
                devletter = "D"
            elif matriz[i][j] == 1:
                devletter = "A"
            elif matriz[i][j] == 2:
                devletter = "B"

            prefix = devletter + "i" + str(int(i)) + "_j" + str(int(j)) + ""
            matplace.add_ports(transistors[i][j].get_ports_list(), prefix=prefix)

    matplace = rename_ports_by_orientation(matplace)

    # Define dictionaries to organize ports by type and orientation
    ports_A = {
        "source_W": [],
        "source_E": [],
        "drain_W": [],
        "drain_E": [],
        "gate_W": [],
        "gate_E": [],
    }
    ports_B = {
        "source_W": [],
        "source_E": [],
        "drain_W": [],
        "drain_E": [],
        "gate_W": [],
        "gate_E": [],
    }
    ports_D = {
        "source_W": [],
        "source_E": [],
        "drain_W": [],
        "drain_E": [],
        "gate_W": [],
        "gate_E": [],
    }

    # List of device types and ports to be searched
    busqueda = [
        ("A", "source"),
        ("A", "drain"),
        ("A", "gate"),
        ("B", "source"),
        ("B", "drain"),
        ("B", "gate"),
        ("D", "source"),
        ("D", "drain"),
        ("D", "gate"),
    ]
    # Cycle through every combination of device and port
    for dispositivo, puerto in busqueda:
        for i in range(len(matriz)):  # Iterate over the matrix rows
            # Get all ports in row i with W and E orientation
            encontrados_W = [
                name
                for name in matplace.ports
                if f"{dispositivo}i{i}" in name
                and f"{puerto}_W" in name
                and "row" not in name
            ]
            encontrados_E = [
                name
                for name in matplace.ports
                if f"{dispositivo}i{i}" in name
                and f"{puerto}_E" in name
                and "row" not in name
            ]
            # Assign the corresponding row only if there are found elements
            if dispositivo == "A":
                if encontrados_W:
                    ports_A[f"{puerto}_W"].append(encontrados_W)
                if encontrados_E:
                    ports_A[f"{puerto}_E"].append(encontrados_E)
            elif dispositivo == "B":
                if encontrados_W:
                    ports_B[f"{puerto}_W"].append(encontrados_W)
                if encontrados_E:
                    ports_B[f"{puerto}_E"].append(encontrados_E)
            elif dispositivo == "D":
                if encontrados_W:
                    ports_D[f"{puerto}_W"].append(encontrados_W)
                if encontrados_E:
                    ports_D[f"{puerto}_E"].append(encontrados_E)

    # Component centering
    matplace_centered = Component()
    matplace_ref = matplace_centered << transformed(prec_ref_center(matplace))
    matplace_centered.add_ports(matplace_ref.get_ports_list())
    dims = evaluate_bbox(matplace_centered)
    xmove = pdk.snap_to_2xgrid(dims[0] / 2)
    if pdk == sky130:
        min_separation = pdk.snap_to_2xgrid(
            (
                pdk.get_grule("met3")["min_separation"]
                + pdk.get_grule("met3")["min_width"]
                + pdk.get_grule("via3")["min_separation"]
                + pdk.get_grule("via3")["min_width"]
            )
        )
    elif pdk == gf180:
        min_separation = pdk.snap_to_2xgrid(
            (
                pdk.get_grule("met3")["min_separation"]
                + pdk.get_grule("met3")["min_width"]
                + pdk.get_grule("via3")["min_separation"]
                + evaluate_bbox(via_stack(pdk, "met2", "met3"))[1]
            )
        )

    # Rings
    # Define configurations according to transistor type
    device_config = {
        "nfet": {
            "sdlayer": "p+s/d",
            "well_layer": "pwell",
            "tap_enclosure_rule": "p+s/d",
        },
        "pfet": {
            "sdlayer": "n+s/d",
            "well_layer": "nwell",
            "tap_enclosure_rule": "n+s/d",
            "substrate_tap_layer": "p+s/d",
        },
    }

    # Obtaining the correct configuration
    config = device_config.get(deviceA_and_B)
    # Add tie if necessary
    if with_tie:
        tie_layers = ["met2", "met1"]

        tap_separation = max(
            pdk.get_grule("met2")["min_separation"],
            pdk.get_grule("met1")["min_separation"],
            pdk.get_grule("active_diff", "active_tap")["min_separation"],
        )
        tap_separation += pdk.get_grule(config["tap_enclosure_rule"], "active_tap")[
            "min_enclosure"
        ]

        tap_encloses = (
            2 * (tap_separation + matplace_centered.xmax),
            2 * (tap_separation + matplace_centered.ymax),
        )
        tapring_ref = matplace_centered << create_tapring_onchip(
            pdk,
            enclosed_rectangle=tap_encloses,
            sdlayer=config["sdlayer"],
            horizontal_glayer=tie_layers[0],
            vertical_glayer=tie_layers[1],
            with_lvt_layer=with_lvt_layer,
        )
        matplace_centered.add_ports(tapring_ref.get_ports_list(), prefix="tie_")
        if with_dummy:
            #first row
            first_mos_ds = matplace_centered.ports["Di0_j0leftsd_array_row0_col0_top_met_W"]
            first_mos_ds.layer = [36,0]
            first_mos_ds_l = matplace_centered.ports["Di0_j0leftsd_array_row0_col0_top_met_E"]
            first_mos_ds_l.layer = [36,0]
            first_mos_gate = matplace_centered.ports["Di0_j0gate_W"]
            first_mos_gate_R = matplace_centered.ports["Di0_j" + str(len(matrizT) - 1) + "gate_E"] 

            #last row
            last_mos_ds = matplace_centered.ports["Di" + str(len(matriz) - 1) + "_j0leftsd_array_row0_col0_top_met_W"]
            last_mos_ds.layer = [36,0]
            last_mos_ds_l = matplace_centered.ports["Di" + str(len(matriz) - 1) + "_j0leftsd_array_row0_col0_top_met_E"]
            last_mos_ds_l.layer = [36,0]
            last_mos_gate = matplace_centered.ports["Di" + str(len(matriz) - 1) + "_j0gate_W"]
            last_mos_gate_R = matplace_centered.ports["Di" + str(len(matriz) - 1) + "_j" + str(len(matrizT) - 1) + "gate_E"]

            tie_left_W = matplace_centered.ports["tie_W_array_row0_col0_top_met_W"]
            tie_right = matplace_centered.ports["tie_E_array_row0_col0_top_met_E"]
            width_route_dummy = 1 if width1 >= 1 else width1
            for i in range(len(matriz)):
                if i == 0:
                    # First Dummys
                    matplace_centered << straight_route(
                        pdk, first_mos_ds_l, tie_left_W, width=width_route_dummy
                    )
                    matplace_centered << straight_route(
                        pdk, first_mos_ds, tie_right, width=width_route_dummy
                    )
                    matplace_centered << straight_route(
                        pdk, first_mos_gate_R, tie_left_W
                    )
                    matplace_centered << straight_route(
                        pdk, first_mos_gate, tie_right
                    )
                elif i == len(matriz) - 1:
                    # Last Dummys
                    matplace_centered << straight_route(
                        pdk, last_mos_ds_l, tie_left_W, width=width_route_dummy
                    )
                    matplace_centered << straight_route(
                        pdk, last_mos_ds, tie_right, width=width_route_dummy
                    )
                    matplace_centered << straight_route(
                        pdk, last_mos_gate_R, tie_left_W
                    )
                    matplace_centered << straight_route(
                        pdk, last_mos_gate, tie_right
                    )
                else:
                    matplace_centered.ports["Di"+ str(i)+ "_j0"+ "row0_col0_rightsd_array_row0_col0_top_met_E"].layer = [36,0]
                    matplace_centered << straight_route(
                        pdk,
                        matplace_centered.ports[
                            "Di"
                            + str(i)
                            + "_j0"
                            + "row0_col0_rightsd_array_row0_col0_top_met_E"
                        ],
                        tie_left_W,
                        width=width_route_dummy,
                    )
                    matplace_centered.ports["Di"+ str(i) + "_j" + str(len(matriz[0]) - 1) + "leftsd_array_row0_col0_top_met_W"].layer = [36,0]
                    matplace_centered << straight_route(
                        pdk,
                        matplace_centered.ports[
                            "Di"
                            + str(i)
                            + "_j"
                            + str(len(matriz[0]) - 1)
                            + "leftsd_array_row0_col0_top_met_W"
                        ],
                        tie_right,
                        width=width_route_dummy,
                    )
                    matplace_centered << straight_route(
                        pdk,
                        matplace_centered.ports["Di" + str(i) + "_j0gate_E"],
                        tie_left_W,
                    )
                    matplace_centered << straight_route(
                        pdk,
                        matplace_centered.ports[
                            "Di" + str(i) + "_j" + str(len(matriz[0]) - 1) + "gate_W"
                        ],
                        tie_right,
                    )
    # Add well
    matplace_centered.add_padding(
        layers=(pdk.get_glayer(config["well_layer"]),),
        default=pdk.get_grule(config["well_layer"], "active_tap")["min_enclosure"],
    )

    # Adding taps on the perimeter
    matplace_centered = add_ports_perimeter(
        matplace_centered, layer=pdk.get_glayer(config["well_layer"]), prefix="well_"
    )
    dims_post_tie = evaluate_bbox(matplace_centered)

    # Add substrate tap if necessary
    if deviceA_and_B == "pfet":
        if with_substrate_tap:
            substrate_tap_separation = pdk.get_grule("dnwell", "active_tap")[
                "min_separation"
            ]
            substrate_tap_encloses = (
                2 * (substrate_tap_separation + matplace_centered.xmax),
                2 * (substrate_tap_separation + matplace_centered.ymax),
            )
            ringtoadd = create_tapring_onchip(
                pdk,
                enclosed_rectangle=substrate_tap_encloses,
                sdlayer=config["substrate_tap_layer"],
                horizontal_glayer="met2",
                vertical_glayer="met1",
                with_lvt_layer=False,
            )
            tapring_ref = matplace_centered << ringtoadd
            matplace_centered.add_ports(
                tapring_ref.get_ports_list(), prefix="substratetap_"
            )

    # Creation of ports and lanes for column routing
    via = via_stack(pdk, "met1", "met2")
    dims = evaluate_bbox(matplace_centered)
    xmove = pdk.snap_to_2xgrid(dims[0] / 2)
    min_separation = pdk.snap_to_2xgrid(
        matplace_centered.ports[ports_A["drain_W"][0][0]].width
        + pdk.get_grule("met3")["min_separation"]
    )
    if enable_B:
        name_vias = [
            ["A_drain_L", -1 * min_separation - xmove],
            ["A_drain_R", 1 * min_separation + xmove],
            ["A_source_L", -2 * min_separation - xmove],
            ["A_source_R", 2 * min_separation + xmove],
            ["A_gate_L", -6 * min_separation - xmove],
            ["A_gate_R", 3 * min_separation + xmove],
            ["B_drain_L", -4 * min_separation - xmove],
            ["B_drain_R", 4 * min_separation + xmove],
            ["B_source_L", -5 * min_separation - xmove],
            ["B_source_R", 5 * min_separation + xmove],
            ["B_gate_L", -3 * min_separation - xmove],
            ["B_gate_R", 6 * min_separation + xmove],
        ]
    else:
        name_vias = [
            ["A_drain_L", -1 * min_separation - xmove],
            ["A_drain_R", 1 * min_separation + xmove],
            ["A_source_L", -2 * min_separation - xmove],
            ["A_source_R", 2 * min_separation + xmove],
            ["A_gate_L", -3 * min_separation - xmove],
            ["A_gate_R", 3 * min_separation + xmove],
        ]

    via_met12 = list()
    via_met23 = list()
    # check if center up and center down transistor are different size
    center_transistor = (len(matriz) // 2, len(matriz) // 2 - 1)
    up_transistors = matriz[center_transistor[0]]
    down_transistors = matriz[center_transistor[1]]
    no_dummys_up = [x for x in up_transistors if x != 0]
    no_dummys_down = [x for x in down_transistors if x != 0]

    if all(x == 1 for x in no_dummys_down) and all(x == 2 for x in no_dummys_up):
        not_middle = True
    elif all(x == 2 for x in no_dummys_down) and all(x == 1 for x in no_dummys_up):
        not_middle = True
    else:
        not_middle = False

    if even and not_middle:
        ypos = (
            devA.ports["source_W"].width * 2 + pdk.get_grule("met2")["min_separation"]
        )
    elif even and not_middle == False:
        ypos = 0
    else:
        center_transistor = len(matriz) // 2
        if with_dummy:
            ypos = (
                matplace_centered.ports[
                    "Di" + str(center_transistor) + "_j0gate_S"
                ].center[1]
                + evaluate_bbox(dummy_single_down)[1] / 2
                + 1 * pdk.get_grule("met2")["min_separation"]
            )
        else:
            if matriz[center_transistor][0] == 1:
                devletter_center = "A"
                ypos = (
                    evaluate_bbox(devA)[1] / 2
                    + 1 * pdk.get_grule("met2")["min_separation"]
                )
            elif matriz[center_transistor][0] == 2:
                devletter_center = "B"
                ypos = (
                    evaluate_bbox(devB)[1] / 2
                    + 3 * pdk.get_grule("met2")["min_separation"]
                )
            ypos += matplace_centered.ports[
                str(devletter_center) + "i" + str(center_transistor) + "_j0gate_S"
            ].center[1]

    for via, pos in name_vias:
        via_met12.append(
            matplace_centered << via_stack(pdk, "met1", "met2", centered=True)
        )
        via_met12[-1].movex(pos)
        via_met12[-1].movey(ypos)
        matplace_centered.add_ports(via_met12[-1].get_ports_list(), prefix=via + "_12_")
        via_met23.append(
            matplace_centered << via_stack(pdk, "met2", "met3", centered=True)
        )
        via_met23[-1].movex(pos)
        via_met23[-1].movey(ypos)
        matplace_centered.add_ports(via_met23[-1].get_ports_list(), prefix=via + "_23_")
    widht_route_vertical = matplace_centered.ports[ports_A["drain_W"][0][0]].width

    for i in range(len(ports_A["drain_E"])):
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["drain_W"][i][0]],
            matplace_centered.ports["A_drain_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["drain_E"][i][0]],
            matplace_centered.ports["A_drain_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["source_W"][i][0]],
            matplace_centered.ports["A_source_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["source_E"][i][0]],
            matplace_centered.ports["A_source_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["gate_W"][i][0]],
            matplace_centered.ports["A_gate_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_A["gate_E"][i][0]],
            matplace_centered.ports["A_gate_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
    for i in range(len(ports_B["drain_E"])):
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["drain_W"][i][0]],
            matplace_centered.ports["B_drain_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["drain_E"][i][0]],
            matplace_centered.ports["B_drain_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["source_W"][i][0]],
            matplace_centered.ports["B_source_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["source_E"][i][0]],
            matplace_centered.ports["B_source_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["gate_W"][i][0]],
            matplace_centered.ports["B_gate_L_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )
        matplace_centered << L_route(
            pdk,
            matplace_centered.ports[ports_B["gate_E"][i][0]],
            matplace_centered.ports["B_gate_R_12_bottom_met_N"],
            hwidth=widht_route_vertical,
        )

    dims = evaluate_bbox(matplace_centered)
    size_out_ports = evaluate_bbox(via_stack(pdk, "met2", "met3"))
    min_separation_met2 = pdk.snap_to_2xgrid(pdk.get_grule("met2")["min_separation"])
    min_separation_via2 = pdk.snap_to_2xgrid(pdk.get_grule("via2")["min_separation"])
    min_separation_met3 = pdk.snap_to_2xgrid(pdk.get_grule("met3")["min_separation"])

    # Gate port 
    gateA = matplace_centered << via_stack(pdk, "met2", "met3")
    gateA.movex(pdk.snap_to_2xgrid(-dims[0] / 2 - size_out_ports[0]/2 - min_separation_met2))
    gateA.movey(ypos)
    matplace_centered.add_ports(gateA.get_ports_list(), prefix="A_gate_")
    if enable_B:
        gateB = matplace_centered << via_stack(pdk, "met2", "met3")
        gateB.movex(pdk.snap_to_2xgrid(dims[0] / 2 + size_out_ports[0]/2 + min_separation_met2))
        gateB.movey(ypos)
        matplace_centered.add_ports(gateB.get_ports_list(), prefix="B_gate_")

    # Source port
    sourceA = matplace_centered << via_stack(pdk, "met2", "met3")
    sourceA.movey(pdk.snap_to_2xgrid(-dims[1] / 2 - size_out_ports[0] / 2 - min_separation_met2))
    sourceA.movex(pdk.snap_to_2xgrid(-min_separation_met3 - size_out_ports[0] / 2 - min_separation_via2))
    matplace_centered.add_ports(sourceA.get_ports_list(), prefix="A_source_")
    if enable_B:
        sourceB = matplace_centered << via_stack(pdk, "met2", "met3")
        sourceB.movey(pdk.snap_to_2xgrid(-dims[1] / 2 - 1.5 * size_out_ports[0] - 2*min_separation_met2))
        sourceB.movex(pdk.snap_to_2xgrid(min_separation_met3 + size_out_ports[0] / 2 + min_separation_via2))
        matplace_centered.add_ports(sourceB.get_ports_list(), prefix="B_source_")

    # Drain port
    drainA = matplace_centered << via_stack(pdk, "met2", "met3")
    drainA.movey(pdk.snap_to_2xgrid(dims[1] / 2 + size_out_ports[0] / 2 + min_separation_met2))
    drainA.movex(pdk.snap_to_2xgrid(-min_separation_met3 - size_out_ports[0] / 2 - min_separation_via2))
    matplace_centered.add_ports(drainA.get_ports_list(), prefix="A_drain_")
    if enable_B:
        drainB = matplace_centered << via_stack(pdk, "met2", "met3")
        drainB.movey(pdk.snap_to_2xgrid(dims[1] / 2 + 1.5 * size_out_ports[0] + 2*min_separation_met2))
        drainB.movex(pdk.snap_to_2xgrid(min_separation_met3 + size_out_ports[0] / 2 + min_separation_via2))
        matplace_centered.add_ports(drainB.get_ports_list(), prefix="B_drain_")

    matplace_centered = rename_ports_by_orientation(matplace_centered)
    # Gates routes
    matplace_centered << straight_route(
        pdk,
        matplace_centered.ports["A_gate_L_23_bottom_met_W"],
        matplace_centered.ports["A_gate_bottom_met_E"],
    )
    if enable_B:
        matplace_centered << straight_route(
            pdk,
            matplace_centered.ports["B_gate_R_23_bottom_met_E"],
            matplace_centered.ports["B_gate_bottom_met_W"],
        )
    # Source routes
    L1 = matplace_centered << L_route(
        pdk,
        matplace_centered.ports["A_source_L_23_top_met_S"],
        matplace_centered.ports["A_source_bottom_met_W"],
        hwidth=widht_route_vertical,
    )
    L2 = matplace_centered << L_route(
        pdk,
        matplace_centered.ports["A_source_R_23_top_met_S"],
        matplace_centered.ports["A_source_bottom_met_E"],
        hwidth=widht_route_vertical,
    )
    if enable_B:
        L3 = matplace_centered << L_route(
            pdk,
            matplace_centered.ports["B_source_L_23_top_met_S"],
            matplace_centered.ports["B_source_bottom_met_W"],
            hwidth=widht_route_vertical,
        )
        L4 = matplace_centered << L_route(
            pdk,
            matplace_centered.ports["B_source_R_23_top_met_S"],
            matplace_centered.ports["B_source_bottom_met_E"],
            hwidth=widht_route_vertical,
        )
    # Drain routes
    L5 = matplace_centered << L_route(
        pdk,
        matplace_centered.ports["A_drain_L_23_top_met_N"],
        matplace_centered.ports["A_drain_bottom_met_W"],
        hwidth=widht_route_vertical,
    )
    L6 = matplace_centered << L_route(
        pdk,
        matplace_centered.ports["A_drain_R_23_top_met_N"],
        matplace_centered.ports["A_drain_bottom_met_E"],
        hwidth=widht_route_vertical,
    )
    if enable_B:
        L7 = matplace_centered << L_route(
            pdk,
            matplace_centered.ports["B_drain_L_23_top_met_N"],
            matplace_centered.ports["B_drain_bottom_met_W"],
            hwidth=widht_route_vertical,
        )
        L8 = matplace_centered << L_route(
            pdk,
            matplace_centered.ports["B_drain_R_23_top_met_N"],
            matplace_centered.ports["B_drain_bottom_met_E"],
            hwidth=widht_route_vertical,
        )

    component = Component()
    component << matplace_centered

    # Get all ports of the original component
    all_ports = matplace_centered.ports
    if enable_B:
        filtros = [
            "A_source_",
            "B_source_",
            "A_drain_",
            "B_drain_",
            "A_gate_",
            "B_gate_",
        ]
    else:
        filtros = ["A_source_", "A_gate_", "A_drain_"]
    # Filter only the ones you need (by name, coordinates, etc.)
    selected_ports = dict()
    for filtro in filtros:
        buscar_w = filtro + "bottom_met_W"
        buscar_e = filtro + "bottom_met_E"
        buscar_n = filtro + "top_met_N"
        buscar_s = filtro + "top_met_S"
        selected_ports = {
            name: port
            for name, port in all_ports.items()
            if buscar_w in name
            or buscar_e in name
            or buscar_n in name
            or buscar_s in name
        }  # Ejemplo: solo los que tienen 'in' en su nombre
        for name, port in selected_ports.items():
            new_name = filtro + name[-1]  # Add prefix
            component.add_port(
                new_name,
                port.center,
                port.width,
                port.orientation,
                layer=port.layer,
                port_type="electrical",
            )
    if with_tie:
        buscar = [
            "tie_N_top_met_W",
            "tie_N_top_met_N",
            "tie_N_top_met_E",
            "tie_N_top_met_S",
            "tie_S_top_met_W",
            "tie_S_top_met_N",
            "tie_S_top_met_E",
            "tie_S_top_met_S",
            "tie_E_top_met_W",
            "tie_E_top_met_N",
            "tie_E_top_met_E",
            "tie_E_top_met_S",
            "tie_W_top_met_W",
            "tie_W_top_met_N",
            "tie_W_top_met_E",
            "tie_W_top_met_S",
        ]
        selected_ports = dict()
        for busqueda in buscar:
            new_port = {
                name: port
                for name, port in all_ports.items()
                if busqueda in name and "row" not in name
            }
            selected_ports.update(new_port)
        for name, port in selected_ports.items():
            posicion = {"N": "up", "S": "down", "E": "right", "W": "left"}
            new_name = "bulk_" + posicion[name[4]] + "_" + name[-1]
            component.add_port(
                new_name,
                port.center,
                port.width,
                port.orientation,
                layer=port.layer,
                port_type="electrical",
            )
    if full_output_size:
        if pdk_sky130:
            ports_list = [
                L1.ports["bottom_layer_W"],
                L1.ports["bottom_layer_N"],
                L2.ports["bottom_layer_E"],
                L2.ports["bottom_layer_S"],
                L5.ports["bottom_layer_W"],
                L5.ports["bottom_layer_N"],
                L6.ports["bottom_layer_E"],
                L6.ports["bottom_layer_S"],
            ]
            names = ["A_source_T_Hor_", "A_drain_T_Hor_"]
            if enable_B:
                ports_list += [
                    L3.ports["bottom_layer_W"],
                    L3.ports["bottom_layer_N"],
                    L4.ports["bottom_layer_E"],
                    L4.ports["bottom_layer_S"],
                    L7.ports["bottom_layer_W"],
                    L7.ports["bottom_layer_N"],
                    L8.ports["bottom_layer_E"],
                    L8.ports["bottom_layer_S"],
                ]
                names += ["B_source_T_Hor_", "B_drain_T_Hor_"]
        elif pdk_gf180:
            ports_list = [
                #A_source_T_Hor_
                L1.ports["bottom_lay_W"],
                L1.ports["bottom_lay_N"],
                L2.ports["bottom_lay_E"],
                L2.ports["bottom_lay_S"],
                #A_drain_T_Hor_
                L5.ports["bottom_lay_W"],
                L5.ports["bottom_lay_N"],
                L6.ports["bottom_lay_E"],
                L6.ports["bottom_lay_S"],
                #A_source_T_Ver_L_
                L1.ports["bottom_lay_W"],
                matplace_centered.ports['A_source_L_23_top_met_N'],
                matplace_centered.ports['A_source_L_23_top_met_E'],
                L1.ports["bottom_lay_S"],
                #A_source_T_Ver_R_
                matplace_centered.ports['A_source_R_23_top_met_W'],
                matplace_centered.ports['A_source_R_23_top_met_N'],
                L2.ports["bottom_lay_E"],
                L2.ports["bottom_lay_S"],
                #A_drain_T_Ver_L_
                matplace_centered.ports['A_drain_L_23_top_met_W'],
                L5.ports["bottom_lay_N"],
                L5.ports["bottom_lay_E"],
                matplace_centered.ports['A_drain_L_23_top_met_S'],
                #A_drain_T_Ver_R_
                L6.ports["bottom_lay_W"],
                L6.ports["bottom_lay_N"],
                matplace_centered.ports['A_drain_R_23_top_met_E'],
                matplace_centered.ports['A_drain_R_23_top_met_S'],
            ]
            names = ["A_source_T_Hor_", "A_drain_T_Hor_", "A_source_T_Ver_L_", "A_source_T_Ver_R_", "A_drain_T_Ver_L_", "A_drain_T_Ver_R_"]
            if enable_B:
                ports_list += [
                    #B_source_T_Hor_
                    L3.ports["bottom_lay_W"],
                    L3.ports["bottom_lay_N"],
                    L4.ports["bottom_lay_E"],
                    L4.ports["bottom_lay_S"],
                    #B_drain_T_Hor_
                    L7.ports["bottom_lay_W"],
                    L7.ports["bottom_lay_N"],
                    L8.ports["bottom_lay_E"],
                    L8.ports["bottom_lay_S"],
                    #B_source_T_Ver_L_
                    L3.ports["bottom_lay_W"],
                    matplace_centered.ports['B_source_L_23_top_met_N'],
                    matplace_centered.ports['B_source_L_23_top_met_E'],
                    L3.ports["bottom_lay_S"],
                    #B_source_T_Ver_R_
                    matplace_centered.ports['B_source_R_23_top_met_W'],
                    matplace_centered.ports['B_source_R_23_top_met_N'],
                    L4.ports["bottom_lay_E"],
                    L4.ports["bottom_lay_S"],
                    #B_drain_T_Ver_L_
                    matplace_centered.ports['B_drain_L_23_top_met_W'],
                    L7.ports["bottom_lay_N"],
                    L7.ports["bottom_lay_E"],
                    matplace_centered.ports['B_drain_L_23_top_met_S'],
                    #B_drain_T_Ver_R_
                    L8.ports["bottom_lay_W"],
                    L8.ports["bottom_lay_N"],
                    matplace_centered.ports['B_drain_R_23_top_met_E'],
                    matplace_centered.ports['B_drain_R_23_top_met_S'],  
                ]
                names += ["B_source_T_Hor_", "B_drain_T_Hor_", "B_source_T_Ver_L_", "B_source_T_Ver_R_", "B_drain_T_Ver_L_", "B_drain_T_Ver_R_"]

        for i in range(len(names)):
            component.add_port(
                names[i] + "W",
                ports_list[4 * i].center,
                ports_list[4 * i].width,
                ports_list[4 * i].orientation,
                layer=ports_list[4 * i].layer,
                port_type="electrical",
            )
            component.add_port(
                names[i] + "N",
                ports_list[4 * i + 1].center,
                ports_list[4 * i + 1].width,
                ports_list[4 * i + 1].orientation,
                layer=ports_list[4 * i + 1].layer,
                port_type="electrical",
            )
            component.add_port(
                names[i] + "E",
                ports_list[4 * i + 2].center,
                ports_list[4 * i + 2].width,
                ports_list[4 * i + 2].orientation,
                layer=ports_list[4 * i + 2].layer,
                port_type="electrical",
            )
            component.add_port(
                names[i] + "S",
                ports_list[4 * i + 3].center,
                ports_list[4 * i + 3].width,
                ports_list[4 * i + 3].orientation,
                layer=ports_list[4 * i + 3].layer,
                port_type="electrical",
            )
    return component_snap_to_grid(component)

The interdigitado_placement_Onchip function also implements a parametric layout generator, in this case designed for interdigitated transistor arrays intended for on-chip design using PDKs such as SkyWater SKY130 and GF180. Unlike macro_two_transistor_placement_Onchip, this function is oriented toward building more general interdigitated structures, where each position in the array can correspond to a specific transistor type (identified by an integer value within an array), thus enabling more complex matching and symmetry patterns.

The output is an object that includes the placement of active transistors, optional dummy devices, bulk/tap rings, and external ports organized according to the position and device type within the array.

In [4]:
def interdigitado_placement_Onchip(
    pdk: MappedPDK,
    deviceA_and_B: Literal["nfet", "pfet"],
    output: Literal["metal", "via"] = "metal",
    output_separation: tuple[Optional[float], Optional[float]] = (0, 0),
    width: float = 1,
    length: float = 2,
    fingers: int = 1,
    with_dummy: bool = False,
    with_lvt_layer: bool = True,
    with_tie: bool = True,
    with_substrate_tap: bool = False,
    gate_common: bool = True,
    routed: bool = False,
    common_route: Optional[Union[bool, tuple[Optional[bool], Optional[bool]]]] = (
        False,
        False,
    ),
    array: list = [[1, 2, 3]],
    **kwargs,
) -> Component:
    """Interdigitated Placement generator
    args:
    pdk = pdk to use
    deviceA_and_B = the device to place for both transistors (either nfet or pfet)
    output = choose the type of output ports between metal or via 
    output_separation = Adds extra spacing to the port position, if routed is active it also modifies the width of the route
    width = Transistor width
    length = Transistor length
    fingers = add extra fingers to transistor
    with_dummy = add dummy transistor arround the component
    with_lvt_layer = add lvt layer
    with_tie = Add Bulk connections
    with_substrate_tap = add substrate tap
    gate_common = allows to separate or connect the transistor's gates
    routed = automatically connects the source and drain of transistors of the same type
    common_route = keeps the drain or source ports (depending on whether they are activated) at the same level in case the common node is required
    array = Devices array for placement

    ports (one port for each edge),
    ****NOTE: source is below component and if with dummys is true remember position in the array has dummys in 0 and -1
    type is the according number in the array
    drain_(position in the array)_(type)_(finger)_... all edges
    source_(position in the array)_(type)_(finger)_... all edges
    if common_gate is true
        gate_l_... all edges
        gate_r_... all edges
    else
        (position in the array)_(type)_gate_... all edges
    bulk_top_... all edges
    bulk_down_... all edges
    bulk_left_... all edges
    bulk_right_... all edges
    """
    interdigitado = Component()
    array = copy.deepcopy(array)
    max_output = max(array[0])
    # Add dummys to array
    if with_dummy:
        column = len(array[0])

        horizontal = [0] * (column + 2)
        array_column = [[0] + row + [0] for row in array]

        array = [horizontal] + array_column + [horizontal]
    arrayT = [list(fila) for fila in zip(*array)]
    # Multiplier's arguments
    kwargs["sdlayer"] = "n+s/d" if deviceA_and_B == "nfet" else "p+s/d"
    kwargs["pdk"] = pdk
    kwargs["dummy"] = (False, False)
    kwargs["routing"] = False
    
    reference = multiplier(
        width=width, length=length, fingers=fingers, gate_down=True, **kwargs
    )
    gate_extension_ref = abs(
        pdk.get_grule("met2")["min_separation"] + reference.ports["gate_W"].width
    )
    if gate_common == False:
        reference = list()
        for i in range(max_output):
            gate_extension = pdk.get_grule("met2")["min_separation"] + gate_extension_ref * i
            kwargs["gate_route_extension"] = pdk.snap_to_2xgrid(gate_extension)
            reference.append(
                multiplier(
                    width=width,
                    length=length,
                    fingers=fingers,
                    gate_down=True,
                    **kwargs,
                )
            )

    # dummy reference
    if with_dummy:
        kwargs["gate_route_extension"] = 0
        dummy_single_up = multiplier(
            width=width, length=length, fingers=1, gate_up=True, **kwargs
        )
        dummy_single_down = multiplier(
            width=width, length=length, fingers=1, gate_down=True, **kwargs
        )
        dummy_up = multiplier(
            width=width, length=length, fingers=fingers, gate_up=True, **kwargs
        )
        dummy_down = multiplier(
            width=width, length=length, fingers=fingers, gate_down=True, **kwargs
        )
    # min separation
    if pdk == sky130:
        min_separation = pdk.get_grule("poly")["min_separation"]
    elif pdk == gf180:
        min_separation = pdk.get_grule("met2")["min_separation"]
    min_separation_met2 = pdk.get_grule("met2")["min_separation"] + 0.01
    min_separation_met3 = pdk.get_grule("met3")["min_separation"] + 0.01
    # Create the array of transistors
    transistors = list()
    for i in range(len(array)):
        transistors_in_row = list()
        for j in range(len(array[i])):
            if i == 0 or i == len(array) - 1:  # first and last row
                if j == 0 or j == len(array[i]) - 1:  # first and last column
                    # corner transistors
                    if array[i][j] == 0 and i == 0:
                        # small dummy
                        transistors_in_row.append(interdigitado << dummy_single_down)
                    elif array[i][j] == 0 and i == len(array) - 1:
                        # small dummy
                        transistors_in_row.append(interdigitado << dummy_single_up)
                    else:
                        if gate_common:
                            transistors_in_row.append(interdigitado << reference)
                        else:
                            transistors_in_row.append(
                                interdigitado << reference[array[i][j] - 1]
                            )
                elif i == 0:  # first row
                    # first row transistors
                    if array[i][j] == 0:
                        # dummy
                        transistors_in_row.append(interdigitado << dummy_down)
                    else:
                        if gate_common:
                            transistors_in_row.append(interdigitado << reference)
                        else:
                            transistors_in_row.append(
                                interdigitado << reference[array[i][j] - 1]
                            )
                else:  # last row
                    # last row transistors
                    if array[i][j] == 0:
                        # dummy
                        transistors_in_row.append(interdigitado << dummy_up)
                    else:
                        if gate_common:
                            transistors_in_row.append(interdigitado << reference)
                        else:
                            transistors_in_row.append(
                                interdigitado << reference[array[i][j] - 1]
                            )
            else:  # middle rows
                if array[i][j] == 0:
                    # small dummy
                    transistors_in_row.append(interdigitado << dummy_single_up)
                else:
                    if gate_common:
                        transistors_in_row.append(interdigitado << reference)
                    else:
                        transistors_in_row.append(
                            interdigitado << reference[array[i][j] - 1]
                        )
        # Add the transistors in the row
        transistors.append(transistors_in_row)
    min_separation_x = pdk.get_grule("p+s/d")["min_separation"] + 0.01
    # [0][1] = distance center to bottom
    # [1][1] = distance center to top
    # Move the transistors
    for i in range(len(transistors)):
        # Move the transistors in y direction
        if i == 0:
            # first row dont move
            ymove = 0
        else:  # find max y size in the row
            distance_center2bottom_ref = transistors[i][0].bbox[0][1]  # Temporal
            distance_center2top_pre_ref = (
                transistors[i - 1][0].bbox[1][1] - ymove
            )  # Temporal // Minus the ymove because this one was already moved
            ymove_temp = (
                abs(distance_center2bottom_ref)
                + abs(distance_center2top_pre_ref)
                + min_separation
            )
            for k in range(len(transistors[i])):
                distance_center2bottom_temp = transistors[i][k].bbox[0][
                    1
                ]  # distance center to bottom of the transistor that will be moved
                distance_center2top_pre_temp = (
                    transistors[i - 1][k].bbox[1][1] - ymove
                )  # distance center to top of the transistor above the one that will be moved
                ymove_temp_2 = (
                    abs(distance_center2bottom_temp)
                    + abs(distance_center2top_pre_temp)
                    + min_separation
                )
                if ymove_temp_2 > ymove_temp:
                    ymove_temp = ymove_temp_2
            ymove += (
                ymove_temp
                if i == 1 or i == len(transistors) - 1
                else ymove_temp + 3 * evaluate_bbox(via_stack(pdk, "met1", "met2"))[1]
            )
        for j in range(len(transistors[i])):
            size_transistor = evaluate_bbox(transistors[i][j])
            # Move the transistors in x direction
            if j == 0:
                # first transistor dont move
                xmove = 0
            else:
                pre_last_size = evaluate_bbox(transistors[i][j - 1])
                # rest of transistors
                xmove += (size_transistor[0] + pre_last_size[0]) / 2 + min_separation_x
            transistors[i][j].movex(pdk.snap_to_2xgrid(round(xmove,2)))
            transistors[i][j].movey(pdk.snap_to_2xgrid(round(ymove,2)))
            interdigitado.add_ports(
                transistors[i][j].get_ports_list(),
                prefix=str(i) + str(j) + "_" + str(array[i][j]) + "_",
            )

    
    # Center the component
    interdigitado = center_component_with_ports(pdk, interdigitado)
    ##RINGS
    # Define configurations according to transistor type
    device_config = {
        "nfet": {
            "sdlayer": "p+s/d",
            "well_layer": None,
            "tap_enclosure_rule": "p+s/d",
        },
        "pfet": {
            "sdlayer": "n+s/d",
            "well_layer": "nwell",
            "tap_enclosure_rule": "n+s/d",
            "substrate_tap_layer": "p+s/d",
        },
    }

    # Obtaining the correct configuration
    config = device_config.get(deviceA_and_B)
    # Add tie if necessary
    if with_tie:
        tie_layers = ["met2", "met1"]

        tap_separation = max(
            pdk.get_grule("met2")["min_separation"],
            pdk.get_grule("met1")["min_separation"],
            pdk.get_grule("active_diff", "active_tap")["min_separation"],
        )
        tap_separation += pdk.get_grule(config["tap_enclosure_rule"], "active_tap")[
            "min_enclosure"
        ]

        tap_encloses = (
            2 * (tap_separation + interdigitado.xmax),
            2 * (tap_separation + interdigitado.ymax),
        )
        tapring_ref = interdigitado << create_tapring_onchip(
            pdk,
            enclosed_rectangle=tap_encloses,
            sdlayer=config["sdlayer"],
            horizontal_glayer=tie_layers[0],
            vertical_glayer=tie_layers[1],
            with_lvt_layer=with_lvt_layer,
        )
        interdigitado.add_ports(tapring_ref.get_ports_list(), prefix="tie_")
        if with_dummy:
                #first row
                first_mos_ds = interdigitado.ports["00_0_leftsd_array_row0_col0_top_met_W"]
                first_mos_ds.layer = [36,0]
                first_mos_ds_l = interdigitado.ports["00_0_leftsd_array_row0_col0_top_met_E"]
                first_mos_ds_l.layer = [36,0]
                first_mos_gate = interdigitado.ports["00_0_gate_W"]
                first_mos_gate_R = interdigitado.ports["0" + str(len(arrayT) - 1) + "_0_gate_E"] 

                #last row
                last_mos_ds = interdigitado.ports[ str(len(array) - 1) + "0_0_leftsd_array_row0_col0_top_met_W"]
                last_mos_ds.layer = [36,0]
                last_mos_ds_l = interdigitado.ports[str(len(array) - 1) + "0_0_leftsd_array_row0_col0_top_met_E"]
                last_mos_ds_l.layer = [36,0]
                last_mos_gate = interdigitado.ports[str(len(array) - 1) + "0_0_gate_W"]
                last_mos_gate_R = interdigitado.ports[str(len(array) - 1) + str(len(arrayT) - 1) + "_0_gate_E"]

                tie_left_W = interdigitado.ports["tie_W_array_row0_col0_top_met_W"]
                tie_right = interdigitado.ports["tie_E_array_row0_col0_top_met_E"]
                width_route_dummy = 1 if width >= 1 else width
                for i in range(len(array)):
                    if i == 0:
                        # First Dummys
                        interdigitado << straight_route(
                            pdk, first_mos_ds_l, tie_left_W, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_ds, tie_right, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_gate_R, tie_left_W
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_gate, tie_right
                        )
                    elif i == len(array) - 1:
                        # Last Dummys
                        interdigitado << straight_route(
                            pdk, last_mos_ds_l, tie_left_W, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_ds, tie_right, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_gate_R, tie_left_W
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_gate, tie_right
                        )
                    else:
                        interdigitado.ports[str(i)+ "0_0_"+ "row0_col0_rightsd_array_row0_col0_top_met_E"].layer = [36,0]
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i)
                                + "0_0_"
                                + "row0_col0_rightsd_array_row0_col0_top_met_E"
                            ],
                            tie_left_W,
                            width=width_route_dummy,
                        )
                        interdigitado.ports[str(i) + str(len(array[0]) - 1) + "_0_leftsd_array_row0_col0_top_met_W"].layer = [36,0]
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i)
                                + str(len(array[0]) - 1)
                                + "_0_leftsd_array_row0_col0_top_met_W"
                            ],
                            tie_right,
                            width=width_route_dummy,
                        )
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[str(i) + "0_0_gate_E"],
                            tie_left_W,
                        )
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i) + str(len(array[0]) - 1) + "_0_gate_W"
                            ],
                            tie_right,
                        )

    # Add well
    if deviceA_and_B == 'pfet':
        # Add well
        interdigitado.add_padding(
            layers=(pdk.get_glayer(config["well_layer"]),),
            default=pdk.get_grule(config["well_layer"], "active_tap")["min_enclosure"],
        )

        # Adding taps on the perimeter
        interdigitado = add_ports_perimeter(
            interdigitado, layer=pdk.get_glayer(config["well_layer"]), prefix="well_"
        )
    dims_post_tie = evaluate_bbox(interdigitado)

    # Add substrate tap if necessary
    if deviceA_and_B == "pfet":
        if with_substrate_tap:
            substrate_tap_separation = pdk.get_grule("dnwell", "active_tap")[
                "min_separation"
            ]
            substrate_tap_encloses = (
                2 * (substrate_tap_separation + interdigitado.xmax),
                2 * (substrate_tap_separation + interdigitado.ymax),
            )
            ringtoadd = create_tapring_onchip(
                pdk,
                enclosed_rectangle=substrate_tap_encloses,
                sdlayer=config["substrate_tap_layer"],
                horizontal_glayer="met2",
                vertical_glayer="met1",
                with_lvt_layer=False,
            )
            tapring_ref = interdigitado << ringtoadd
            interdigitado.add_ports(
                tapring_ref.get_ports_list(), prefix="substratetap_"
            )
    # Output port
    T_not_dummy = 0
    size_interdigitado = evaluate_bbox(interdigitado)
    
    for i in range(len(array)):
        for j in range(len(array[i])):
            if array[i][j] == 0:
                continue
            else:
                T_not_dummy += 1
                port_reference_top = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_leftsd_top_met_N"
                ]
                port_reference_bottom = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_leftsd_top_met_S"
                ]
                port_referenceg_left = (
                    interdigitado.ports["11_" + str(array[1][1]) + "_gate_W"]
                    if with_dummy
                    else interdigitado.ports["00_" + str(array[0][0]) + "_gate_W"]
                )
                port_referenceg_right = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_gate_E"
                ]
                # port_reference_top.width = port_reference_bottom.width
                rect = rectangle(
                    (port_reference_top.width, port_reference_bottom.width),
                    layer=pdk.get_glayer("met3"),
                    centered = True
                )
                via = via_stack(pdk, "met2", "met3")
                output_port = rect if output == "metal" else via
                size_rect = evaluate_bbox(rect)
                size_via = evaluate_bbox(via)
                size_output = size_rect if output == "metal" else size_via
                salidas_row = list()
                drain = 0
                source = 0
                for k in range(fingers + 1):
                    salidas_row.append(interdigitado << output_port)
                    reference = (port_reference_top if k % 2 == 0 else port_reference_bottom)
                    separation = output_separation[0] + size_output[1] + min_separation_met2 if k%2 == 0 else output_separation[1] + size_output[1] + min_separation_met2
                    xmove = (reference.center[0])
                    ymove = (size_interdigitado[1]/2 + size_output[1]/2 + min_separation_met2 + output_separation[0] +(separation*(array[i][j]-1)))
                    if k%2 == 1:
                        ymove -= output_separation[0]
                        ymove += output_separation[1]
                        ymove = -1*ymove
                    if common_route[0] and k % 2 == 0:
                        ymove -= separation * (array[i][j]-1)
                    elif common_route[1] and k % 2 == 1:
                        ymove += separation * (array[i][j]-1)
                    salidas_row[-1].movex(pdk.snap_to_2xgrid(round(xmove,2)))
                    salidas_row[-1].movey(pdk.snap_to_2xgrid(round(ymove,2)))
                    if k%2 == 0:
                        output_port_name = "e2" if output == "metal" else "top_met_N" 
                    else :
                        output_port_name = "e4" if output == "metal" else "top_met_S" 

                    # print(salidas_row[-1].get_ports_list())
                    route = interdigitado << straight_route(
                        pdk,
                        salidas_row[-1].ports[output_port_name],
                        reference,
                        glayer1="met3",
                        glayer2="met2",
                    )
                    prefix = (
                        "drain_"
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_"
                        + str(drain)
                        + "_"
                        if k % 2 == 0
                        else "source_"
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_"
                        + str(source)
                        + "_"
                    )
                    interdigitado.add_ports(
                        salidas_row[-1].get_ports_list(), prefix=prefix
                    )
                    interdigitado.add_ports(
                        route.get_ports_list(), prefix=prefix
                    )
                    if k == fingers:
                        break
                    drain += 1 if k % 2 == 0 else 0
                    source += 1 if k % 2 == 1 else 0
                    port_reference_top = interdigitado.ports[
                        str(i)
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_row0_col"
                        + str(k)
                        + "_rightsd_top_met_S"
                    ]
                    port_reference_bottom = interdigitado.ports[
                        str(i)
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_row0_col"
                        + str(k)
                        + "_rightsd_top_met_N"
                    ]
    if gate_common:
        salidas_gate = list()
        for i in range(2):
            salidas_gate.append(interdigitado << output_port)
            referenceg = port_referenceg_left if i == 0 else port_referenceg_right
            xmove = pdk.snap_to_2xgrid(size_interdigitado[0]/2 + size_output[0]/2 + min_separation_met3)
            ymove = pdk.snap_to_2xgrid(referenceg.center[1])
            if i == 0:
                xmove = -1*xmove            
            salidas_gate[-1].movex(round(xmove,2))
            salidas_gate[-1].movey(round(ymove,2))
            prefix = "gate1_" if i == 0 else "gate2_"
            interdigitado.add_ports(salidas_gate[-1].get_ports_list(), prefix=prefix)
        interdigitado = rename_ports_by_orientation(interdigitado)
        ports_gate = (
            ["gate2_E", "gate1_W"]
            if output == "metal"
            else ["gate2_bottom_met_E", "gate1_bottom_met_W"]
        )
        interdigitado << straight_route(
            pdk,
            interdigitado.ports[ports_gate[0]],
            interdigitado.ports[ports_gate[1]],
            glayer1="met2",
            glayer2="met2",
        )
    # routing common nodes
    if routed:
        positions = {}
        #search initial and last position of each transistor in the array
        array_busqueda = array[1] if with_dummy else array[0]
        for i, num in enumerate(array_busqueda):
            if num not in positions:
                positions[num] = [i, i]  
            else:
                positions[num][1] = i
        routes = list()
        ports_routed = list()
        name_ports_routed = list()
        for transistor in positions:
            if transistor != 0:
                if positions[transistor][0] == positions[transistor][1]:
                    continue
                if output == 'via':
                    firts_port_drain = interdigitado.ports['drain_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_bottom_met_W']
                    last_port_drain =  interdigitado.ports['drain_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_bottom_met_E']
                    firts_port_source = interdigitado.ports['source_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_bottom_met_W']
                    last_port_source =  interdigitado.ports['source_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_bottom_met_E']
                else:
                    firts_port_drain = interdigitado.ports['drain_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_W']
                    last_port_drain =  interdigitado.ports['drain_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_E']
                    firts_port_source = interdigitado.ports['source_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_W']
                    last_port_source =  interdigitado.ports['source_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_E']
                #route ports
                routes.append(interdigitado << straight_route(pdk, firts_port_drain, last_port_drain, width = output_separation[0]))
                routes.append(interdigitado << straight_route(pdk, firts_port_source, last_port_source, width = output_separation[1]))
                #save ports
                interdigitado.add_ports(routes[-2].ports, prefix='route_drain_'+str(transistor)+'_')
                interdigitado.add_ports(routes[-1].ports, prefix='route_source_'+str(transistor)+'_')
                ports_routed.append('route_drain_'+str(transistor)+'_route_')
                ports_routed.append('route_source_'+str(transistor)+'_route_')
                name_ports_routed.append('route_drain_'+str(transistor)+'_')
                name_ports_routed.append('route_source_'+str(transistor)+'_')

    # Save ports
    component = Component()
    component << interdigitado
    all_ports = interdigitado.ports

    ports = list()

    if with_tie:
        buscar = [
            "tie_N_top_met_W",
            "tie_N_top_met_N",
            "tie_N_top_met_E",
            "tie_N_top_met_S",
            "tie_S_top_met_W",
            "tie_S_top_met_N",
            "tie_S_top_met_E",
            "tie_S_top_met_S",
            "tie_E_top_met_W",
            "tie_E_top_met_N",
            "tie_E_top_met_E",
            "tie_E_top_met_S",
            "tie_W_top_met_W",
            "tie_W_top_met_N",
            "tie_W_top_met_E",
            "tie_W_top_met_S",
        ]
        selected_ports = dict()
        for busqueda in buscar:
            new_port = {
                name: port
                for name, port in all_ports.items()
                if busqueda in name and "row" not in name
            }
            selected_ports.update(new_port)
        for name, port in selected_ports.items():
            posicion = {"N": "up", "S": "down", "E": "right", "W": "left"}
            new_name = "bulk_" + posicion[name[4]] + "_" + name[-1]
            component.add_port(
                new_name,
                port.center,
                port.width,
                port.orientation,
                layer=port.layer,
                port_type="electrical",
            )
    
    interdigitado =  (rename_ports_by_orientation(interdigitado))
    
    if routed:
        for i in range(len(ports_routed)):
            filtrar_puertos(interdigitado, component, ports_routed[i], name_ports_routed[i])


    ports = list()
    name = list()
    for i in range(len(array)):
        for j in range(len(array[i])):
            if array[i][j] == 0:
                continue
            else:
                drain = 0
                source = 0
                for k in range(fingers + 1):
                    if k % 2 == 0:
                        if output == "metal":
                            ports.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(drain)
                                + "_"
                            )
                            name.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(drain)
                                + "_"
                            )
                        elif output == "via":
                            ports.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(drain)
                                + "_top_met_"
                            )
                            name.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(drain)
                                + "_"
                            )
                        ports.append(
                            "drain_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(drain)
                            + "_route_"
                        )
                        name.append(
                            "drain_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(drain)
                            + "_route_"
                        )
                        drain += 1
                        
                    else:
                        if output == "metal":
                            ports.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(source)
                                + "_"
                            )
                            name.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(source)
                                + "_"
                            )
                        elif output == "via":
                            ports.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(source)
                                + "_top_met_"
                            )
                            name.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(source)
                                + "_"
                            )
                        ports.append(
                            "source_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(source)
                            + "_route_"
                        )
                        name.append(
                            "source_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(source)
                            + "_route_"
                        )
                        source += 1
    if gate_common:
        gate_names = (
            ["gate1_", "gate2_"]
            if output == "metal"
            else ["gate1_top_met_", "gate2_top_met_"]
        )
        ports.append(gate_names[0])
        ports.append(gate_names[1])
        name.append("gate1_")
        name.append("gate2_")
    else:
        all_ports = interdigitado.ports
        selected_ports = {
            name: port
            for name, port in all_ports.items()
            if "gate" in name and "row" not in name and "_0_" not in name
        }
        for name_original, port in selected_ports.items():
            new_name = name_original[1:]
            component.add_port(
                new_name,
                port.center,
                port.width,
                port.orientation,
                layer=port.layer,
                port_type="electrical",
            )
    
    # Add ports to component
    for i in range(len(ports)):
        filtrar_puertos(interdigitado, component, ports[i], name[i])
    # port name format
    # source/drain + position + type transistor + output number(if there are more than one finger)
    # port name format common gate
    # gate1_ left gate_2 right
    # port name format not common gate
    # postion + type transistor + gate + direction
    # center component
    # component = center_component_with_ports(component)
    return component_snap_to_grid(component)  # return interdigitado

The interdigitado_cascode_placement_Onchip function implements a parametric layout generator specifically designed for interdigitated arrays in a cascode configuration, distinguishing itself from macro_two_transistor_placement_Onchip and interdigitado_placement_Onchip in both placement topology and the exposure of external terminals.

Starting from a base matrix that defines the types of transistors in a single row, the function duplicates this structure vertically to form two stacked device levels (lower and upper). On this foundation, the cascode architecture is constructed: the inner rows serve as the coupling region between the two levels, while the outer rows are reserved for the external terminals: source in the lower row and drain in the upper row.

In [5]:
def interdigitado_cascode_placement_Onchip(
    pdk: MappedPDK,
    deviceA_and_B: Literal["nfet", "pfet"],
    output: Literal["metal", "via"] = "metal",
    output_separation: tuple[Optional[float], Optional[float]] = (0, 0),
    width: float = 1,
    length: float = 2,
    fingers: int = 1,
    with_dummy: bool = False,
    with_lvt_layer: bool = True,
    with_tie: bool = True,
    with_substrate_tap: bool = False,
    common_route: Optional[Union[bool, tuple[Optional[bool], Optional[bool]]]] = (
        False,
        False,
    ),
    routed: bool = False,
    array: list = [[1, 2, 3]],
    **kwargs,
) -> Component:
    """Interdigitated Placement generator
    args:
    pdk = pdk to use
    deviceA_and_B = the device to place for both transistors (either nfet or pfet)
    output = choose the type of output ports between metal or via 
    output_separation = Adds extra spacing to the port position, if routed is active it also modifies the width of the route
    width = Transistor width
    length = Transistor length
    fingers = add extra fingers to transistor
    with_dummy = add dummy transistor arround the component
    with_lvt_layer = add lvt layer
    with_tie = Add Bulk connections
    with_substrate_tap = add substrate tap
    common_route = keeps the drain or source ports (depending on whether they are activated) at the same level in case the common node is required
    routed = automatically connects the source and drain of transistors of the same type
    array = Devices array for placement

    ports (one port for each edge),
    ****NOTE: source is below component and if with dummys is true remember position in the array has dummys in 0 and -1
    type is the according number in the array
    drain_(position in the placement col)_(type)_(finger)_... all edges
    source_(position in the placement col)_(type)_(finger)_... all edges
    gate_l_(row position)_... all edges
    gate_r_(row position)... all edges
    bulk_top_... all edges
    bulk_down_... all edges
    bulk_left_... all edges
    bulk_right_... all edges
    """
    interdigitado = Component()
    max_array = max(array[0])
    array = copy.deepcopy(array)
    if output != "metal" and output != "via":
        raise ValueError("Output must be metal or via")
    # Duplicate the array
    array = array * 2
    # Add dummys to array
    if with_dummy:
        column = len(array[0])

        horizontal = [0] * (column + 2)
        array_column = [[0] + row + [0] for row in array]

        array = [horizontal] + array_column + [horizontal]
    arrayT = [list(fila) for fila in zip(*array)]
    # Multiplier's arguments
    kwargs["sdlayer"] = "n+s/d" if deviceA_and_B == "nfet" else "p+s/d"
    kwargs["pdk"] = pdk
    kwargs["dummy"] = (False, False)
    kwargs["routing"] = False
    kwargs["gate_route_extension"] = abs(pdk.get_grule("met2")["min_separation"])    
    reference = multiplier(
        width=width, length=length, fingers=fingers, gate_down=True, **kwargs
    )
    # dummy reference
    if with_dummy:
        dummy_single_up = multiplier(
            width=width, length=length, fingers=1, gate_up=True, **kwargs
        )
        dummy_single_down = multiplier(
            width=width, length=length, fingers=1, gate_down=True, **kwargs
        )
        dummy_up = multiplier(
            width=width, length=length, fingers=fingers, gate_up=True, **kwargs
        )
        dummy_down = multiplier(
            width=width, length=length, fingers=fingers, gate_down=True, **kwargs
        )
    # min separation
    if pdk == sky130:
        min_separation = pdk.get_grule("poly")["min_separation"]
    elif pdk == gf180:
        min_separation = pdk.get_grule("met2")["min_separation"]
    # Create the array of transistors
    transistors = list()
    for i in range(len(array)):
        transistors_in_row = list()
        for j in range(len(array[i])):
            if i == 0 or i == len(array) - 1:  # first and last row
                if j == 0 or j == len(array[i]) - 1:  # first and last column
                    # corner transistors
                    if array[i][j] == 0 and i == 0:
                        # small dummy
                        transistors_in_row.append(interdigitado << dummy_single_down)
                    elif array[i][j] == 0 and i == len(array) - 1:
                        # small dummy
                        transistors_in_row.append(interdigitado << dummy_single_up)
                    else:
                        transistors_in_row.append(interdigitado << reference)
                elif i == 0:  # first row
                    # first row transistors
                    if array[i][j] == 0:
                        # dummy
                        transistors_in_row.append(interdigitado << dummy_down)
                    else:
                        transistors_in_row.append(interdigitado << reference)
                else:  # last row
                    # last row transistors
                    if array[i][j] == 0:
                        # dummy
                        transistors_in_row.append(interdigitado << dummy_up)
                    else:
                        transistors_in_row.append(interdigitado << reference)
            else:  # middle rows
                if array[i][j] == 0:
                    # small dummy
                    transistors_in_row.append(interdigitado << dummy_single_up)
                else:
                    transistors_in_row.append(interdigitado << reference)
        # Add the transistors in the row
        transistors.append(transistors_in_row)
    min_separation_x = pdk.get_grule("p+s/d")["min_separation"] + 0.01
    min_separation_met2 = pdk.get_grule("met2")["min_separation"] + 0.01
    min_separation_met3 = pdk.get_grule("met3")["min_separation"] + 0.01
    # [0][1] = distance center to bottom
    # [1][1] = distance center to top
    # Move the transistors
    for i in range(len(transistors)):
        # Move the transistors in y direction
        if i == 0:
            # first row dont move
            ymove = 0
        else:  # find max y size in the row
            distance_center2bottom_ref = transistors[i][0].bbox[0][1]  # Temporal
            distance_center2top_pre_ref = (
                transistors[i - 1][0].bbox[1][1] - ymove
            )  # Temporal // Minus the ymove because this one was already moved
            ymove_temp = (
                abs(distance_center2bottom_ref)
                + abs(distance_center2top_pre_ref)
                + min_separation
            )
            for k in range(len(transistors[i])):
                distance_center2bottom_temp = transistors[i][k].bbox[0][
                    1
                ]  # distance center to bottom of the transistor that will be moved
                distance_center2top_pre_temp = (
                    transistors[i - 1][k].bbox[1][1] - ymove
                )  # distance center to top of the transistor above the one that will be moved
                ymove_temp_2 = (
                    abs(distance_center2bottom_temp)
                    + abs(distance_center2top_pre_temp)
                    + min_separation
                )
                if ymove_temp_2 > ymove_temp:
                    ymove_temp = ymove_temp_2
            ymove += (
                ymove_temp
                if i == 1 or i == len(transistors) - 1
                else ymove_temp
                + 3 * evaluate_bbox(via_stack(pdk, "met1", "met2"))[1]
                + (evaluate_bbox(via_stack(pdk, "met1", "met2"))[1] * (max_array - 1))
            )
        for j in range(len(transistors[i])):
            size_transistor = evaluate_bbox(transistors[i][j])
            # Move the transistors in x direction
            if j == 0:
                # first transistor dont move
                xmove = 0
            else:
                pre_last_size = evaluate_bbox(transistors[i][j - 1])
                # rest of transistors
                xmove += (size_transistor[0] + pre_last_size[0]) / 2 + min_separation_x
            transistors[i][j].movex(pdk.snap_to_2xgrid(round(xmove,2)))
            transistors[i][j].movey(pdk.snap_to_2xgrid(round(ymove,2)))

            interdigitado.add_ports(
                transistors[i][j].get_ports_list(),
                prefix=str(i) + str(j) + "_" + str(array[i][j]) + "_",
            )
    # Center the component
    interdigitado = center_component_with_ports(pdk, interdigitado)
    ##RINGS
    # Define configurations according to transistor type
    device_config = {
        "nfet": {
            "sdlayer": "p+s/d",
            "well_layer": "pwell",
            "tap_enclosure_rule": "p+s/d",
        },
        "pfet": {
            "sdlayer": "n+s/d",
            "well_layer": "dnwell",
            "tap_enclosure_rule": "n+s/d",
            "substrate_tap_layer": "p+s/d",
        },
    }

    # Obtaining the correct configuration
    config = device_config.get(deviceA_and_B)
    # Add tie if necessary
    if with_tie:
        tie_layers = ["met2", "met1"]

        tap_separation = max(
            pdk.get_grule("met2")["min_separation"],
            pdk.get_grule("met1")["min_separation"],
            pdk.get_grule("active_diff", "active_tap")["min_separation"],
        )
        tap_separation += pdk.get_grule(config["tap_enclosure_rule"], "active_tap")[
            "min_enclosure"
        ]

        tap_encloses = (
            2 * (tap_separation + interdigitado.xmax),
            2 * (tap_separation + interdigitado.ymax),
        )
        tapring_ref = interdigitado << create_tapring_onchip(
            pdk,
            enclosed_rectangle=tap_encloses,
            sdlayer=config["sdlayer"],
            horizontal_glayer=tie_layers[0],
            vertical_glayer=tie_layers[1],
            with_lvt_layer=with_lvt_layer,
        )
        interdigitado.add_ports(tapring_ref.get_ports_list(), prefix="tie_")
        if with_dummy:
                #first row
                first_mos_ds = interdigitado.ports["00_0_leftsd_array_row0_col0_top_met_W"]
                first_mos_ds.layer = [36,0]
                first_mos_ds_l = interdigitado.ports["00_0_leftsd_array_row0_col0_top_met_E"]
                first_mos_ds_l.layer = [36,0]
                first_mos_gate = interdigitado.ports["00_0_gate_W"]
                first_mos_gate_R = interdigitado.ports["0" + str(len(arrayT) - 1) + "_0_gate_E"] 

                #last row
                last_mos_ds = interdigitado.ports[ str(len(array) - 1) + "0_0_leftsd_array_row0_col0_top_met_W"]
                last_mos_ds.layer = [36,0]
                last_mos_ds_l = interdigitado.ports[str(len(array) - 1) + "0_0_leftsd_array_row0_col0_top_met_E"]
                last_mos_ds_l.layer = [36,0]
                last_mos_gate = interdigitado.ports[str(len(array) - 1) + "0_0_gate_W"]
                last_mos_gate_R = interdigitado.ports[str(len(array) - 1) + str(len(arrayT) - 1) + "_0_gate_E"]

                tie_left_W = interdigitado.ports["tie_W_array_row0_col0_top_met_W"]
                tie_right = interdigitado.ports["tie_E_array_row0_col0_top_met_E"]
                width_route_dummy = 1 if width >= 1 else width
                for i in range(len(array)):
                    if i == 0:
                        # First Dummys
                        interdigitado << straight_route(
                            pdk, first_mos_ds_l, tie_left_W, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_ds, tie_right, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_gate_R, tie_left_W
                        )
                        interdigitado << straight_route(
                            pdk, first_mos_gate, tie_right
                        )
                    elif i == len(array) - 1:
                        # Last Dummys
                        interdigitado << straight_route(
                            pdk, last_mos_ds_l, tie_left_W, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_ds, tie_right, width=width_route_dummy
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_gate_R, tie_left_W
                        )
                        interdigitado << straight_route(
                            pdk, last_mos_gate, tie_right
                        )
                    else:
                        interdigitado.ports[str(i)+ "0_0_"+ "row0_col0_rightsd_array_row0_col0_top_met_E"].layer = [36,0]
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i)
                                + "0_0_"
                                + "row0_col0_rightsd_array_row0_col0_top_met_E"
                            ],
                            tie_left_W,
                            width=width_route_dummy,
                        )
                        interdigitado.ports[str(i) + str(len(array[0]) - 1) + "_0_leftsd_array_row0_col0_top_met_W"].layer = [36,0]
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i)
                                + str(len(array[0]) - 1)
                                + "_0_leftsd_array_row0_col0_top_met_W"
                            ],
                            tie_right,
                            width=width_route_dummy,
                        )
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[str(i) + "0_0_gate_E"],
                            tie_left_W,
                        )
                        interdigitado << straight_route(
                            pdk,
                            interdigitado.ports[
                                str(i) + str(len(array[0]) - 1) + "_0_gate_W"
                            ],
                            tie_right,
                        )
    if deviceA_and_B == 'pfet':
        # Add well
        interdigitado.add_padding(
            layers=(pdk.get_glayer(config["well_layer"]),),
            default=pdk.get_grule(config["well_layer"], "active_tap")["min_enclosure"],
        )

        # Adding taps on the perimeter
        interdigitado = add_ports_perimeter(
            interdigitado, layer=pdk.get_glayer(config["well_layer"]), prefix="well_"
        )
    dims_post_tie = evaluate_bbox(interdigitado)

    # Add substrate tap if necessary
    if deviceA_and_B == "pfet":
        if with_substrate_tap:
            substrate_tap_separation = pdk.get_grule("dnwell", "active_tap")[
                "min_separation"
            ]
            substrate_tap_encloses = (
                2 * (substrate_tap_separation + interdigitado.xmax),
                2 * (substrate_tap_separation + interdigitado.ymax),
            )
            ringtoadd = create_tapring_onchip(
                pdk,
                enclosed_rectangle=substrate_tap_encloses,
                sdlayer=config["substrate_tap_layer"],
                horizontal_glayer="met2",
                vertical_glayer="met1",
                with_lvt_layer=False,
            )
            tapring_ref = interdigitado << ringtoadd
            interdigitado.add_ports(
                tapring_ref.get_ports_list(), prefix="substratetap_"
            )
    # Outputs and routing
    size_interdigitado = evaluate_bbox(interdigitado)
    T_not_dummy = 0
    up = False
    down = False
    salidas_gate = list()

    for i in range(len(array)):
        for j in range(len(array[i])):
            if (i == 1 and with_dummy) or (i == 0 and with_dummy == False):
                down = True
                up = False
            elif (i == len(array) - 2 and with_dummy) or (
                i == len(array) - 1 and with_dummy == False
            ):
                up = True
                down = False
            else:
                up = False
                down = False

            if array[i][j] == 0:
                continue
            else:
                T_not_dummy += 1
                size_transistor = evaluate_bbox(transistors[i][j])
                port_reference_top = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_leftsd_top_met_S"
                ]
                port_reference_bottom = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_leftsd_top_met_N"
                ]
                port_referenceg_left = (
                    interdigitado.ports["11_" + str(array[1][1]) + "_gate_W"]
                    if with_dummy
                    else interdigitado.ports["00_" + str(array[0][0]) + "_gate_W"]
                )
                port_referenceg_right = interdigitado.ports[
                    str(i) + str(j) + "_" + str(array[i][j]) + "_gate_E"
                ]
                rect = rectangle(
                    (port_reference_top.width, port_reference_bottom.width),
                    layer=pdk.get_glayer("met3"),
                    centered = True
                )
                rect_hor = rectangle(
                    (port_reference_top.width, port_reference_bottom.width),
                    layer=pdk.get_glayer("met2"),
                )
                via = via_stack(pdk, "met2", "met3")
                via_hor = via_stack(pdk, "met1", "met2")
                output_port = rect if output == "metal" else via
                rectg = rectangle(
                    (port_referenceg_left.width, port_referenceg_right.width),
                    layer=pdk.get_glayer("met2"),
                )
                size_rect = evaluate_bbox(rect)
                size_rectg = evaluate_bbox(rectg)
                size_via = evaluate_bbox(via)
                size_output = size_rect if output == "metal" else size_via
                size_via_hor = evaluate_bbox(via_hor)
                salidas_row = list()
                middle_port = list()
                drain = 0
                source = 0
                for k in range(fingers + 1):
                    if up and k % 2 == 0:
                        salidas_row.append(interdigitado << output_port)
                        reference = port_reference_top
                        xmove = port_reference_top.center[0]
                        salidas_row[-1].movex(pdk.snap_to_2xgrid(round(xmove,2)))
                        distance_out_ring = (size_interdigitado[1] / 2 + min_separation_met2 + size_output[1]/2)
                        separation = output_separation[0] + size_output[1] + min_separation_met2
                        ymove = distance_out_ring + output_separation[0] + separation * (array[i][j]-1)
                        if common_route[0] and k % 2 == 0:
                            ymove -= separation * (array[i][j] - 1)
                        salidas_row[-1].movey(pdk.snap_to_2xgrid(ymove))
                        output_port_name = "e2" if output == "metal" else "top_met_S"
                        route = interdigitado << straight_route(
                            pdk,
                            salidas_row[-1].ports[output_port_name],
                            reference,
                            glayer1="met3",
                            glayer2="met2",
                        )
                        prefix = (
                            "drain_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(drain)
                            + "_"
                        )
                        interdigitado.add_ports(
                            salidas_row[-1].get_ports_list(), prefix=prefix
                        )
                        interdigitado.add_ports(
                            route.get_ports_list(), prefix=prefix
                        )
                        drain += 1
                    elif up and k % 2 == 1:
                        middle_port.append(interdigitado << via_hor)
                        move_middle_port = [
                            port_ruteo_top.center[0],
                            port_gate_top.center[1]
                            - (size_output[1] + size_via_hor[1]) / 2
                            - min_separation_met2,
                        ]
                        middle_port[-1].movex(
                            pdk.snap_to_2xgrid(round(move_middle_port[0],2))
                        ).movey(pdk.snap_to_2xgrid(round(move_middle_port[1],2)))
                        extra_movey = (min_separation_met2 + size_via_hor[1]) * (
                            array[i][j] - 1
                        )
                        middle_port[-1].movey(pdk.snap_to_2xgrid(-extra_movey))
                        interdigitado << straight_route(
                            pdk, port_ruteo_top, port_ruteo_bot
                        )
                        interdigitado.add_ports(
                            middle_port[-1].get_ports_list(),
                            prefix="middle_"
                            + str(i)
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(k)
                            + "_",
                        )

                    elif down and k % 2 == 0:
                        salidas_row.append(interdigitado << output_port)
                        reference = port_reference_bottom
                        xmove = port_reference_bottom.center[0]
                        salidas_row[-1].movex(pdk.snap_to_2xgrid(round(xmove,2)))
                        distance_out_ring = (size_interdigitado[1] / 2 + min_separation_met2 + size_output[1]/2)
                        separation = output_separation[1] + size_output[1] + min_separation_met2
                        ymove = -1 * (distance_out_ring + output_separation[1] + separation * (array[i][j]-1))
                        if common_route[1] and k % 2 == 0:
                            ymove += separation * (array[i][j]-1)
                        salidas_row[-1].movey(pdk.snap_to_2xgrid(round(ymove,2)))
                        output_port_name = "e2" if output == "metal" else "top_met_S"
                        route = interdigitado << straight_route(
                            pdk,
                            salidas_row[-1].ports[output_port_name],
                            reference,
                            glayer1="met3",
                            glayer2="met2",
                        )
                        prefix = (
                            "source_"
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_"
                            + str(source)
                            + "_"
                        )
                        interdigitado.add_ports(
                            salidas_row[-1].get_ports_list(), prefix=prefix
                        )
                        interdigitado.add_ports(
                            route.get_ports_list(), prefix=prefix
                        )
                        source += 1
                    if k == fingers:
                        break
                    port_reference_top = interdigitado.ports[
                        str(i)
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_row0_col"
                        + str(k)
                        + "_rightsd_top_met_N"
                    ]
                    port_reference_bottom = interdigitado.ports[
                        str(i)
                        + str(j)
                        + "_"
                        + str(array[i][j])
                        + "_row0_col"
                        + str(k)
                        + "_rightsd_top_met_S"
                    ]
                    if up:
                        port_ruteo_top = interdigitado.ports[
                            str(i)
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_row0_col"
                            + str(k)
                            + "_rightsd_top_met_S"
                        ]
                        port_gate_top = interdigitado.ports[
                            str(i) + str(j) + "_" + str(array[i][j]) + "_gate_E"
                        ]
                        port_ruteo_bot = interdigitado.ports[
                            str(i - 1)
                            + str(j)
                            + "_"
                            + str(array[i][j])
                            + "_row0_col"
                            + str(k)
                            + "_rightsd_top_met_S"
                        ]
    rows = len(array)
    cols = len(array[0])
    output_port = rect_hor if output == "metal" else via
    # Ruteo intermedio
    # ports_name = [name for name in interdigitado.ports if "middle" in name]
    for i in range(max_array + 1):
        port_inicial = [
            name
            for name in interdigitado.ports
            if "middle_" in name
            and "_" + str(i) + "_1_" in name
            and "top_met_E" in name
        ]
        if len(port_inicial) > 1:
            interdigitado << straight_route(
                pdk,
                interdigitado.ports[port_inicial[0]],
                interdigitado.ports[port_inicial[-1]],
            )

    # Ruteo gate
    for i in range(rows):
        if ((i > 0 and i < rows - 1) and with_dummy) or with_dummy == False:
            port_reference_left = (interdigitado.ports[str(i) + "1_" + str(array[1][1]) + "_gate_W"] if with_dummy
                else interdigitado.ports[str(i) + "0_" + str(array[0][0]) + "_gate_W"]
            )
            port_reference_right = (interdigitado.ports[str(i) + str(cols - 2) + "_" + str(array[i][cols - 2]) + "_gate_E"] if with_dummy
                else interdigitado.ports[
                    str(i) + str(cols - 1) + "_" + str(array[i][cols - 1]) + "_gate_E"
                ]
            )
            salidas_gate.append(interdigitado << output_port)
            salidas_gate.append(interdigitado << output_port)
            
            salidas_gate[-1].movey(pdk.snap_to_2xgrid(round(port_reference_left.center[1],2)))
            salidas_gate[-1].movex(pdk.snap_to_2xgrid(round(-size_interdigitado[0]/2 - min_separation_met3 - size_output[0]/2,2)))
            salidas_gate[-2].movey(pdk.snap_to_2xgrid(round(port_reference_right.center[1],2)))
            salidas_gate[-2].movex(pdk.snap_to_2xgrid(round(size_interdigitado[0]/2 + min_separation_met3 + size_output[0]/2,2)))
            
            # prefix = 'gate1_' if i==0 else 'gate2_'
            prefix_left = "gate_" + str(i) + "_l_"
            prefix_right = "gate_" + str(i) + "_r_"
            interdigitado.add_ports(
                salidas_gate[-1].get_ports_list(), prefix=prefix_left
            )
            interdigitado.add_ports(
                salidas_gate[-2].get_ports_list(), prefix=prefix_right
            )
            interdigitado = rename_ports_by_orientation(interdigitado)
            ports_gate = (
                ["gate_" + str(i) + "_l_E", "gate_" + str(i) + "_r_W"]
                if output == "metal"
                else [
                    "gate_" + str(i) + "_l_bottom_met_E",
                    "gate_" + str(i) + "_r_bottom_met_W",
                ]
            )
            interdigitado << straight_route(
                pdk,
                interdigitado.ports[ports_gate[0]],
                interdigitado.ports[ports_gate[1]],
                glayer1="met2",
                glayer2="met2",
            )

    # Ruteo salidas
    if routed:
        positions = {}
        #search initial and last position of each transistor in the array
        array_busqueda = array[1] if with_dummy else array[0]
        for i, num in enumerate(array_busqueda):
            if num not in positions:
                positions[num] = [i, i]  
            else:
                positions[num][1] = i
        routes = list()
        ports_routed = list()
        name_ports_routed = list()
        for transistor in positions:
            if transistor != 0:
                if output == 'via':
                    firts_port_drain = interdigitado.ports['drain_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_bottom_met_W']
                    last_port_drain =  interdigitado.ports['drain_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_bottom_met_E']
                    firts_port_source = interdigitado.ports['source_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_bottom_met_W']
                    last_port_source =  interdigitado.ports['source_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_bottom_met_E']
                else:
                    firts_port_drain = interdigitado.ports['drain_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_e1']
                    last_port_drain =  interdigitado.ports['drain_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_e3']
                    firts_port_source = interdigitado.ports['source_' + str(positions[transistor][0]) + '_' + str(array_busqueda[positions[transistor][0]]) + '_0_e1']
                    last_port_source =  interdigitado.ports['source_' + str(positions[transistor][1]) + '_' + str(array_busqueda[positions[transistor][1]]) + '_0_e3']
                #route ports
                routes.append(interdigitado << straight_route(pdk, firts_port_drain, last_port_drain, width = output_separation[0]))
                routes.append(interdigitado << straight_route(pdk, firts_port_source, last_port_source, width = output_separation[1]))
                #save ports
                interdigitado.add_ports(routes[-2].ports, prefix='route_drain_'+str(transistor)+'_')
                interdigitado.add_ports(routes[-1].ports, prefix='route_source_'+str(transistor)+'_')
                ports_routed.append('route_drain_'+str(transistor)+'_route_')
                ports_routed.append('route_source_'+str(transistor)+'_route_')
                name_ports_routed.append('route_drain_'+str(transistor)+'_')
                name_ports_routed.append('route_source_'+str(transistor)+'_')    

    # Save ports
    component = Component()
    component << interdigitado
    all_ports = interdigitado.ports

    ports = list()

    if with_tie:
        buscar = [
            "tie_N_top_met_W",
            "tie_N_top_met_N",
            "tie_N_top_met_E",
            "tie_N_top_met_S",
            "tie_S_top_met_W",
            "tie_S_top_met_N",
            "tie_S_top_met_E",
            "tie_S_top_met_S",
            "tie_E_top_met_W",
            "tie_E_top_met_N",
            "tie_E_top_met_E",
            "tie_E_top_met_S",
            "tie_W_top_met_W",
            "tie_W_top_met_N",
            "tie_W_top_met_E",
            "tie_W_top_met_S",
        ]
        selected_ports = dict()
        for busqueda in buscar:
            new_port = {
                name: port
                for name, port in all_ports.items()
                if busqueda in name and "row" not in name
            }
            selected_ports.update(new_port)
        for name, port in selected_ports.items():
            posicion = {"N": "up", "S": "down", "E": "right", "W": "left"}
            new_name = "bulk_" + posicion[name[4]] + "_" + name[-1]
            component.add_port(
                new_name,
                port.center,
                port.width,
                port.orientation,
                layer=port.layer,
                port_type="electrical",
            )

    ports = list()
    name = list()
    for i in range(len(array)):
        for j in range(len(array[i])):
            if array[i][j] == 0:
                continue
            else:
                out_source = 0
                out_drain = 0
                if (i == 1 and with_dummy) or (
                    i == 0 and with_dummy == False
                ):  # or i==rows-1)
                    for k in range(fingers + 1):
                        if k % 2 == 0:
                            if output == "metal":
                                ports.append(
                                    "source_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_source)
                                    + "_"
                                )
                                name.append(
                                    "source_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_source)
                                    + "_"
                                )
                            elif output == "via":
                                ports.append(
                                    "source_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_source)
                                    + "_top_met_"
                                )
                                name.append(
                                    "source_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_source)
                                    + "_"
                                )
                            ports.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(out_source)
                                + "_route_"
                            )
                            name.append(
                                "source_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(out_source)
                                + "_route_"
                            )
                            out_source += 1
                if (i == rows - 2 and with_dummy) or (
                    i == rows - 1 and with_dummy == False
                ):
                    for k in range(fingers + 1):
                        if k % 2 == 0:
                            if output == "metal":
                                ports.append(
                                    "drain_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_drain)
                                    + "_"
                                )
                                name.append(
                                    "drain_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_drain)
                                    + "_"
                                )
                            elif output == "via":
                                ports.append(
                                    "drain_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_drain)
                                    + "_top_met_"
                                )
                                name.append(
                                    "drain_"
                                    + str(j)
                                    + "_"
                                    + str(array[i][j])
                                    + "_"
                                    + str(out_drain)
                                    + "_"
                                )
                            ports.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(out_drain)
                                + "_route_"
                            )
                            name.append(
                                "drain_"
                                + str(j)
                                + "_"
                                + str(array[i][j])
                                + "_"
                                + str(out_drain)
                                + "_route_"
                            )
                            out_drain += 1

    for i in range(rows):
        if ((i > 0 and i < rows - 1) and with_dummy) or with_dummy == False:
            name_gate = (
                ["gate_" + str(i) + "_l_", "gate_" + str(i) + "_r_"]
                if output == "metal"
                else [
                    "gate_" + str(i) + "_l_top_met_",
                    "gate_" + str(i) + "_r_top_met_",
                ]
            )
            ports.append(name_gate[0])
            ports.append(name_gate[1])
            name.append("gate_" + str(i) + "_l_")
            name.append("gate_" + str(i) + "_r_")

    if routed:
        for i in range(len(ports_routed)):
            filtrar_puertos(interdigitado, component, ports_routed[i], name_ports_routed[i])


    for i in range(len(ports)):
        filtrar_puertos(interdigitado, component, ports[i], name[i], signal=False)
    # port name format
    # source/drain + position + type transistor + output number(if there are more than one finger)
    # gate + position + l/r
    # center component
    component = center_component_with_ports(pdk, component)
    return component_snap_to_grid(component)  # return interdigitado

# Auxiliary functions

The transistor placement process is supported by the following set of auxiliary functions:

    • create_tapring_onchip 
    • multiplier 
    • layer_pin_and_label 
    • pin_label_creation 
    • filtrar_puertos 
    • center_component_with_ports 
    • Boundary_layer 
    • power_rails_placement 

Below is a brief description of each of these functions:

**create_tapring_onchip**

Adapted from the original [tapring](https://github.com/ReaLLMASIC/gLayout/blob/main/src/glayout/primitives/guardring.py) function in Glayout, this function generates a rectangular ring of taps surrounding a specified area, in full compliance with the PDK’s design rules. It creates the active tap regions, doping layers (sdlayer), via arrays toward horizontal and vertical metal layers, and L-shaped corner connections, while adding ports on all four sides of the ring. Optionally, it can include specific layers for LVT devices in technologies such as Sky130.

**Multiplier**

Adapted from the [multiplier](https://github.com/ReaLLMASIC/gLayout/blob/main/src/glayout/primitives/fet.py) function in Glayout, this function constructs a parameterized transistor based on the PDK, the source/drain layer, the width, length, and number of fingers. It can automatically route gates, sources, and drains using upper metal layers, control the width and extension of the routes, and add lateral dummy regions with their corresponding connections. The function returns a component with standardized ports for gate, source, drain, diffusion, and doping.

**layer_pin_and_label**

Returns the physical layer (layer number and purpose) associated with pins or labels for a given metal, according to the selected PDK. Based on the logical name of the metal layer and the requested type (“label” or “pin”), it queries technology-specific internal dictionaries and provides the correct layer for layout generation.

**pin_label_creation**

Creates, over an existing component port, the pin geometry (when applicable) and text label corresponding to a specific net. It references the port, determines the pin and label layers according to the metal and PDK, places a pin rectangle centered on the port, and adds a label at its center. Optionally, it prints to the console information about the pin and label creation.

**filtrar_puertos**

Copies a set of ports from an original component to a target component according to a provided name prefix. It identifies the port variants with orientation suffixes (W, E, N, S), replicates their position, size, orientation, and layer, and assigns them new names based on the given prefix.

**center_component_with_ports**

Re-centers a component around the coordinate origin, simultaneously adjusting the position of all its ports. It calculates the required displacement, moves the geometry accordingly, and rebuilds the ports with updated coordinates while maintaining their electrical properties. The function returns a new, centered component ready for integration into higher-level hierarchies.

**Boundary_layer**

Creates a boundary layer that completely encloses the component, using the appropriate layer defined by the PDK. It evaluates the dimensions of the component, draws a centered rectangle with those dimensions on the boundary layer, and inserts it into the component. This envelope explicitly defines the physical limits of the cell.

**power_rails_placement**

Generates power rails (horizontal or vertical) over a component using upper metal layers, with width and spacing calculated to meet design rules. Each rail is assigned a label (defaulting to VDD/VSS or a custom list), and, if requested, pins and labels are added. The function can automatically connect component ports to the rails using via arrays, verifying that sufficient space is available for these connections.



In [6]:
def create_tapring_onchip(
    pdk: MappedPDK,
    enclosed_rectangle=(2.0, 4.0),
    sdlayer: str = "p+s/d",
    horizontal_glayer: str = "met2",
    vertical_glayer: str = "met1",
    sides: tuple[bool, bool, bool, bool] = (True, True, True, True),
    with_lvt_layer=False,  # New input variable
) -> Component:
    """ptapring produce a p substrate / pwell tap rectanglular ring
    This ring will legally enclose a rectangular shape
    args:
    pdk: MappedPDK is the pdk to use
    enclosed_rectangle: tuple is the (width, hieght) of the area to enclose
    ****NOTE: the enclosed_rectangle will be the enclosed dimensions of active_tap
    horizontal_glayer: string=met2, layer used over the ring horizontally
    vertical_glayer: string=met1, layer used over the ring vertically
    sides: instead of creating the ring on all sides, only create it on the specified sides (W,N,E,S)
    ports:
    Narr_... all ports in top via array
    Sarr_... all ports in bottom via array
    Earr_... all ports in right via array
    Warr_... all ports in left via array
    bl_corner_...all ports in bottom left L route
    """
    enclosed_rectangle = pdk.snap_to_2xgrid(enclosed_rectangle, return_type="float")
    # check layers, activate pdk, create top cell
    pdk.has_required_glayers(
        [sdlayer, "active_tap", "mcon", horizontal_glayer, vertical_glayer]
    )
    pdk.activate()
    ptapring = Component()
    if not "met" in horizontal_glayer or not "met" in vertical_glayer:
        raise ValueError("both horizontal and vertical glayers should be metals")
    # check that ring is not too small
    min_gap_tap = pdk.get_grule("active_tap")["min_separation"]
    if enclosed_rectangle[0] < min_gap_tap:
        raise ValueError("ptapring must be larger than " + str(min_gap_tap))
    # create active tap
    tap_width = max(
        pdk.get_grule("active_tap")["min_width"],
        2 * pdk.get_grule("active_tap", "mcon")["min_enclosure"]
        + pdk.get_grule("mcon")["width"],
    )
    ptapring << rectangular_ring(
        enclosed_size=enclosed_rectangle,
        width=tap_width,
        centered=True,
        layer=pdk.get_glayer("active_tap"),
    )
    # create p plus area
    pp_enclosure = pdk.get_grule("active_tap", sdlayer)["min_enclosure"]
    pp_width = 2 * pp_enclosure + tap_width
    pp_enclosed_rectangle = [dim - 2 * pp_enclosure for dim in enclosed_rectangle]
    ptapring << rectangular_ring(
        enclosed_size=pp_enclosed_rectangle,
        width=pp_width,
        centered=True,
        layer=pdk.get_glayer(sdlayer),
    )

    ###########################################################################################################################################################
    # Create a LVT layer for LVT transistors from schematic design
    if pdk is sky130:
        # create 65/44 area
        con = (65, 44)
        ptapring << rectangular_ring(
            enclosed_size=enclosed_rectangle,
            width=tap_width,
            centered=True,
            layer=con,
        )

        if with_lvt_layer:
            # create lvt area for nmos
            lvt_layer = (125, 44)
            ptapring << rectangle(
                size=enclosed_rectangle,
                centered=True,
                layer=lvt_layer,
            )
    ###########################################################################################################################################################

    # create via arrs
    via_width_horizontal = evaluate_bbox(
        via_stack(pdk, "active_tap", horizontal_glayer)
    )[0]
    arr_size_horizontal = enclosed_rectangle[0]
    horizontal_arr = via_array(
        pdk,
        "active_tap",
        horizontal_glayer,
        (arr_size_horizontal, via_width_horizontal),
        minus1=True,
        lay_every_layer=True,
    )
    # Create via vertical
    via_width_vertical = evaluate_bbox(via_stack(pdk, "active_tap", vertical_glayer))[1]
    arr_size_vertical = enclosed_rectangle[1]
    vertical_arr = via_array(
        pdk,
        "active_tap",
        vertical_glayer,
        (via_width_vertical, arr_size_vertical),
        minus1=True,
        lay_every_layer=True,
    )

    # add via arrs
    refs_prefixes = list()
    if sides[1]:
        metal_ref_n = ptapring << horizontal_arr
        metal_ref_n.movey(round(0.5 * (enclosed_rectangle[1] + tap_width), 4))
        refs_prefixes.append((metal_ref_n, "N_"))
    if sides[2]:
        metal_ref_e = ptapring << vertical_arr
        metal_ref_e.movex(round(0.5 * (enclosed_rectangle[0] + tap_width), 4))
        refs_prefixes.append((metal_ref_e, "E_"))
    if sides[3]:
        metal_ref_s = ptapring << horizontal_arr
        metal_ref_s.movey(round(-0.5 * (enclosed_rectangle[1] + tap_width), 4))
        refs_prefixes.append((metal_ref_s, "S_"))
    if sides[0]:
        metal_ref_w = ptapring << vertical_arr
        metal_ref_w.movex(round(-0.5 * (enclosed_rectangle[0] + tap_width), 4))
        refs_prefixes.append((metal_ref_w, "W_"))
    # connect vertices
    if sides[1] and sides[0]:
        tlvia = ptapring << L_route(
            pdk, metal_ref_n.ports["top_met_W"], metal_ref_w.ports["top_met_N"]
        )
        refs_prefixes += [(tlvia, "tl_")]
    if sides[1] and sides[2]:
        trvia = ptapring << L_route(
            pdk, metal_ref_n.ports["top_met_E"], metal_ref_e.ports["top_met_N"]
        )
        refs_prefixes += [(trvia, "tr_")]
    if sides[3] and sides[0]:
        blvia = ptapring << L_route(
            pdk, metal_ref_s.ports["top_met_W"], metal_ref_w.ports["top_met_S"]
        )
        refs_prefixes += [(blvia, "bl_")]
    if sides[3] and sides[2]:
        brvia = ptapring << L_route(
            pdk, metal_ref_s.ports["top_met_E"], metal_ref_e.ports["top_met_S"]
        )
        refs_prefixes += [(brvia, "br_")]
    # add ports, flatten and return
    for ref_, prefix in refs_prefixes:
        ptapring.add_ports(ref_.get_ports_list(), prefix=prefix)
    return component_snap_to_grid(ptapring)

# drain is above source
def multiplier(
    pdk: MappedPDK,
    sdlayer: str,
    width: Optional[float] = 3,
    length: Optional[float] = None,
    fingers: int = 1,
    routing: bool = True,
    inter_finger_topmet: str = "met2",
    dummy: Union[bool, tuple[bool, bool]] = True,
    sd_route_topmet: str = "met2",
    gate_route_topmet: str = "met2",
    rmult: Optional[int] = None,
    sd_rmult: int = 1,
    gate_rmult: int = 1,
    interfinger_rmult: int = 1,
    sd_route_extension: float = 0,
    gate_route_extension: float = 0,
    dummy_routes: bool = True,
    gate_up: Optional[bool] = False,
    gate_down: Optional[bool] = False,
) -> Component:
    """Generic poly/sd vias generator
    args:
    pdk = pdk to use
    sdlayer = either p+s/d for pmos or n+s/d for nmos
    width = expands the transistor in the y direction
    length = transitor length (if left None defaults to min length)
    fingers = introduces additional fingers (sharing s/d) of width=width
    routing = true or false, specfies if sd should be connected
    inter_finger_topmet = top metal of the via array laid on the source/drain regions
    ****NOTE: routing metal is layed over the source drain regions regardless of routing option
    dummy = true or false add dummy active/plus doped regions
    sd_rmult = multiplies thickness of sd metal (int only)
    gate_rmult = multiplies gate by adding rows to the gate via array (int only)
    interfinger_rmult = multiplies thickness of source/drain routes between the gates (int only)
    sd_route_extension = float, how far extra to extend the source/drain connections (default=0)
    gate_route_extension = float, how far extra to extend the gate connection (default=0)
    dummy_routes: bool default=True, if true add add vias and short dummy poly,source,drain

    ports (one port for each edge),
    ****NOTE: source is below drain:
    gate_... all edges (top met route of gate connection)
    source_...all edges (top met route of source connections)
    drain_...all edges (top met route of drain connections)
    plusdoped_...all edges (area of p+s/d or n+s/d layer)
    diff_...all edges (diffusion region)
    rowx_coly_...all ports associated with finger array include gate_... and array_ (array includes all ports of the viastacks in the array)
    leftsd_...all ports associated with the left most via array
    dummy_L,R_N,E,S,W ports if dummy_routes=True
    """
    # error checking
    if "+s/d" not in sdlayer:
        raise ValueError("specify + doped region for multiplier")
    if not "met" in sd_route_topmet or not "met" in gate_route_topmet:
        raise ValueError("topmet specified must be metal layer")
    if rmult:
        if rmult < 1:
            raise ValueError("rmult must be positive int")
        sd_rmult = rmult
        gate_rmult = 1
        interfinger_rmult = (rmult - 1) or 1
    if sd_rmult < 1 or interfinger_rmult < 1 or gate_rmult < 1:
        raise ValueError("routing multipliers must be positive int")
    if fingers < 1:
        raise ValueError("number of fingers must be positive int")

    ###########################################################################################################################################################
    # Conditions to avoid double overlapping or duplication of gates in dummies
    if gate_up and gate_down:
        raise ValueError("Gate up and Down can't be at the same time")
    if routing and (gate_down or gate_up):
        raise ValueError("Gate up and Down can't be used with routing")
    ###########################################################################################################################################################

    # argument parsing and rule setup
    min_length = pdk.get_grule("poly")["min_width"]
    length = min_length if (length or min_length) <= min_length else length
    length = pdk.snap_to_2xgrid(length)
    min_width = max(min_length, pdk.get_grule("active_diff")["min_width"])
    width = min_width if (width or min_width) <= min_width else width
    width = pdk.snap_to_2xgrid(width)
    poly_height = width + 2 * pdk.get_grule("poly", "active_diff")["overhang"]
    # call finger array
    multiplier = __gen_fingers_macro(
        pdk,
        interfinger_rmult,
        fingers,
        length,
        width,
        poly_height,
        sdlayer,
        inter_finger_topmet,
    )
    # route all drains/ gates/ sources
    if routing:
        # place vias, then straight route from top port to via-botmet_N
        sd_N_port = multiplier.ports["leftsd_top_met_N"]
        sdvia = via_stack(pdk, "met1", sd_route_topmet)
        sdmet_hieght = sd_rmult * evaluate_bbox(sdvia)[1]
        sdroute_minsep = pdk.get_grule(sd_route_topmet)["min_separation"]
        sdvia_ports = list()
        for finger in range(fingers + 1):
            diff_top_port = movey(sd_N_port, destination=width / 2)
            # place sdvia such that metal does not overlap diffusion
            big_extension = sdroute_minsep + sdmet_hieght / 2 + sdmet_hieght
            sdvia_extension = big_extension if finger % 2 else sdmet_hieght / 2
            sdvia_ref = align_comp_to_port(sdvia, diff_top_port, alignment=("c", "t"))
            multiplier.add(
                sdvia_ref.movey(
                    sdvia_extension + pdk.snap_to_2xgrid(sd_route_extension)
                )
            )
            multiplier << straight_route(
                pdk, diff_top_port, sdvia_ref.ports["bottom_met_N"]
            )
            sdvia_ports += [sdvia_ref.ports["top_met_W"], sdvia_ref.ports["top_met_E"]]
            # get the next port (break before this if last iteration because port D.N.E. and num gates=fingers)
            if finger == fingers:
                break
            sd_N_port = multiplier.ports[f"row0_col{finger}_rightsd_top_met_N"]
            # route gates
            gate_S_port = multiplier.ports[f"row0_col{finger}_gate_S"]
            metal_seperation = pdk.util_max_metal_seperation()
            psuedo_Ngateroute = movey(
                gate_S_port.copy(), 0 - metal_seperation - gate_route_extension
            )
            psuedo_Ngateroute.y = pdk.snap_to_2xgrid(psuedo_Ngateroute.y)
            multiplier << straight_route(pdk, gate_S_port, psuedo_Ngateroute)
        # place route met: gate
        gate_width = (
            gate_S_port.center[0]
            - multiplier.ports["row0_col0_gate_S"].center[0]
            + gate_S_port.width
        )
        gate = rename_ports_by_list(
            via_array(
                pdk,
                "poly",
                gate_route_topmet,
                size=(gate_width, None),
                num_vias=(None, gate_rmult),
                no_exception=True,
                fullbottom=True,
            ),
            [("top_met_", "gate_")],
        )
        gate_ref = align_comp_to_port(
            gate.copy(),
            psuedo_Ngateroute,
            alignment=(None, "b"),
            layer=pdk.get_glayer("poly"),
        )
        multiplier.add(gate_ref)
        # place route met: source, drain
        sd_width = sdvia_ports[-1].center[0] - sdvia_ports[0].center[0]
        sd_route = rectangle(
            size=(sd_width, sdmet_hieght),
            layer=pdk.get_glayer(sd_route_topmet),
            centered=True,
        )
        source = align_comp_to_port(
            sd_route.copy(), sdvia_ports[0], alignment=(None, "c")
        )
        drain = align_comp_to_port(
            sd_route.copy(), sdvia_ports[2], alignment=(None, "c")
        )
        multiplier.add(source)
        multiplier.add(drain)
        # add ports
        multiplier.add_ports(drain.get_ports_list(), prefix="drain_")
        multiplier.add_ports(source.get_ports_list(), prefix="source_")
        multiplier.add_ports(gate_ref.get_ports_list(prefix="gate_"))

    ###########################################################################################################################################################
    # Added the option to place the gate above or below the component along with its connection ports as long as routing = False.
    if gate_down:
        for finger in range(fingers):
            gate_S_port = multiplier.ports[f"row0_col{finger}_gate_S"]
            metal_seperation = pdk.util_max_metal_seperation()
            psuedo_Ngateroute = movey(
                gate_S_port.copy(), 0 - metal_seperation - gate_route_extension
            )
            psuedo_Ngateroute.y = pdk.snap_to_2xgrid(psuedo_Ngateroute.y)
            multiplier << straight_route(pdk, gate_S_port, psuedo_Ngateroute)
        gate_width = (
            gate_S_port.center[0]
            - multiplier.ports["row0_col0_gate_S"].center[0]
            + gate_S_port.width
        )
        gate = rename_ports_by_list(
            via_array(
                pdk,
                "poly",
                gate_route_topmet,
                size=(gate_width, None),
                num_vias=(None, gate_rmult),
                no_exception=True,
                fullbottom=True,
            ),
            [("top_met_", "gate_")],
        )
        gate_ref = align_comp_to_port(
            gate.copy(),
            psuedo_Ngateroute,
            alignment=(None, "b"),
            layer=pdk.get_glayer("poly"),
        )
        multiplier.add(gate_ref)
        multiplier.add_ports(gate_ref.get_ports_list(prefix="gate_"))
    elif gate_up:
        for finger in range(fingers):
            gate_N_port = multiplier.ports[f"row0_col{finger}_gate_N"]
            metal_seperation = pdk.util_max_metal_seperation()
            psuedo_Ngateroute = movey(
                gate_N_port.copy(), 0 + metal_seperation + gate_route_extension
            )
            psuedo_Ngateroute.y = pdk.snap_to_2xgrid(psuedo_Ngateroute.y)
            multiplier << straight_route(pdk, gate_N_port, psuedo_Ngateroute)
        gate_width = (
            gate_N_port.center[0]
            - multiplier.ports["row0_col0_gate_N"].center[0]
            + gate_N_port.width
        )
        gate = rename_ports_by_list(
            via_array(
                pdk,
                "poly",
                gate_route_topmet,
                size=(gate_width, None),
                num_vias=(None, gate_rmult),
                no_exception=True,
                fullbottom=True,
            ),
            [("top_met_", "gate_")],
        )
        gate_ref = align_comp_to_port(
            gate.copy(),
            psuedo_Ngateroute,
            alignment=(None, "t"),
            layer=pdk.get_glayer("poly"),
        )
        multiplier.add(gate_ref)
        multiplier.add_ports(gate_ref.get_ports_list(prefix="gate_"))
    ###########################################################################################################################################################

    # create dummy regions
    if isinstance(dummy, bool):
        dummyl = dummyr = dummy
    else:
        dummyl, dummyr = dummy
    if dummyl or dummyr:
        dummy = __gen_fingers_macro(
            pdk,
            rmult=interfinger_rmult,
            fingers=1,
            length=length,
            width=width,
            poly_height=poly_height,
            sdlayer=sdlayer,
            inter_finger_topmet="met1",
        )
        dummyvia = dummy << via_stack(pdk, "poly", "met1", fullbottom=True)
        align_comp_to_port(
            dummyvia, dummy.ports["row0_col0_gate_S"], layer=pdk.get_glayer("poly")
        )
        dummy << L_route(
            pdk, dummyvia.ports["top_met_W"], dummy.ports["leftsd_top_met_S"]
        )
        dummy << L_route(
            pdk, dummyvia.ports["top_met_E"], dummy.ports["row0_col0_rightsd_top_met_S"]
        )
        dummy.add_ports(dummyvia.get_ports_list(), prefix="gsdcon_")
        dummy_space = pdk.get_grule(sdlayer)["min_separation"] + dummy.xmax
        sides = list()
        if dummyl:
            sides.append((-1, "dummy_L_"))
        if dummyr:
            sides.append((1, "dummy_R_"))
        for side, name in sides:
            dummy_ref = multiplier << dummy
            dummy_ref.movex(side * (dummy_space + multiplier.xmax))
            multiplier.add_ports(dummy_ref.get_ports_list(), prefix=name)
    return component_snap_to_grid(rename_ports_by_orientation(multiplier))


def layer_pin_and_label(pdk:MappedPDK, metal: str, label_or_pin: str):
    """pin and label dictionary
    returns the pin or label layer according to the metal specified
    args:
    pdk = pdk to use
    metal = metal in which the pin is located
    lbael_or_pin = choose between returning the pin or label layer
    """
    if not "met" in metal:
        raise ValueError("layer must be a metal")
    if label_or_pin not in ["label", "pin"]:
        raise ValueError("label_or_pin must be 'label' or 'pin'")

    if pdk is sky130:
        diccionario_label = {
            "met1": (67, 5),
            "met2": (68, 5),
            "met3": (69, 5),
            "met4": (70, 5),
            "met5": (71, 5),
        }
        diccionario_pin = {
            "met1": (67, 16),
            "met2": (68, 16),
            "met3": (69, 16),
            "met4": (70, 16),
            "met5": (71, 16),
        }
    
    elif pdk is gf180:
        diccionario_label = {
            "met1": (34, 10),
            "met2": (36, 10),
            "met3": (42, 10),
            "met4": (46, 10),
            "met5": (81, 10),
        }
        diccionario_pin = {
            "met1": (67, 16),
            "met2": (68, 16),
            "met3": (69, 16),
            "met4": (70, 16),
            "met5": (71, 16),
        }
    if label_or_pin == "label":
        layer = diccionario_label[metal]
    else:
        layer = diccionario_pin[metal]
    return layer


def pin_label_creation(pdk:MappedPDK, port, label, met, componente, signal: bool = False):
    """pin and/or label creator
    creates the pin layer (only in sky130) and/or label in a port
    args:
    pdk = pdk to use
    port = reference port
    label = label you want to add
    met = metal on which the label and pin will be added
    componente = component to which the label and pin is to be added
    signal = flag to print creation singal in the console
    """
    # Obtengo el ancho del port en x e y
    x_size = componente.ports[port + "_N"].width
    y_size = componente.ports[port + "_W"].width
    label_met = layer_pin_and_label(pdk, met, "label")
    pin_met = layer_pin_and_label(pdk, met, "pin")
    # Obtengo la posicion central del port
    pos = [
        componente.ports[port + "_N"].center[0],
        componente.ports[port + "_E"].center[1],
    ]
    # Calculo el centro del rectangulo con la layer del pian a agregar
    center = [pos[0] - y_size / 2, pos[1] - y_size / 2]
    # Creo el rectangulo para pin
    if pdk is sky130:
        pin_rectangle = rectangle(size=(y_size, y_size), layer=pin_met)
        # Agrego el pin y lo centro
        pin_t = componente << pin_rectangle
        pl = pin_t.bbox
        offset = -pl[0]
        pin_t.move(destination=offset)
        # Lo ubico a la posicion final calculada
        pin_t.movey(center[1]).movex(center[0])
        # Agrego los ports al componente
        componente.add_ports(pin_t.get_ports_list(), prefix=label + "_")
    # Agrego el label segun el metal
    componente.add_label(label, position=(pos[0], pos[1]), layer=label_met)
    if signal:
        print(f"Pin {port} and label {label} created on component with metal {met}.")


def filtrar_puertos(
    componente_original,
    componente_filtrado,
    filtro,
    port_name: Optional[str] = None,
    signal: bool = False,
    ):
    """filtrar puertos
    Function that allows you to save the ports indicated from one component to another    
    args:
    componente_original = Original component that contains all ports
    componente_filtrado = Destination component that saves the ports
    filtro = port names (end the name with _)
    port_name = new name for the original port. If none will keep original
    signal = flag to print filtered port in the console
    """
    if port_name is None:
        port_name = filtro
    all_ports = componente_original.ports
    buscar_w = filtro + "W"
    buscar_e = filtro + "E"
    buscar_n = filtro + "N"
    buscar_s = filtro + "S"
    if buscar_w not in all_ports:
        raise ValueError(f"Port not found")
    selected_ports = {
        name: port
        for name, port in all_ports.items()
        if buscar_w in name or buscar_e in name or buscar_n in name or buscar_s in name
    }  # Ejemplo: solo los que tienen 'in' en su nombre
    for name_original, port in selected_ports.items():
        new_name = port_name + name_original[-1]  # Add prefix
        componente_filtrado.add_port(
            new_name,
            port.center,
            port.width,
            port.orientation,
            layer=port.layer,
            port_type="electrical",
        )
    if signal:
        print(f"Port {port_name} filtered and added to the component.")


def center_component_with_ports(pdk, component: Component) -> Component:
    centered = Component()
    ref = centered << component

    # Calcular el desplazamiento necesario para centrar
    dx, dy = pdk.snap_to_2xgrid(-component.center[0]), pdk.snap_to_2xgrid(-component.center[1])
    ref.move((dx, dy))  # Mueve la referencia al centro

    # Transformar y añadir los puertos
    for port in component.get_ports_list():
        new_port = port.copy()
        new_port.center = (port.center[0] + dx, port.center[1] + dy)
        centered.add_port(name=port.name, port=new_port)

    return centered


def Boundary_layer(pdk:MappedPDK, componente=Component(), layer=(235, 4)) -> Component:
    """Boundary_layer
    Function that creates the boundary layer   
    args:
    pdk = pdk to use
    componente = component to which the layer is added
    layer = optional to add a different layer
    """
    if pdk is sky130:
        layer=(235, 4)
    elif pdk is gf180:
        layer=(63,0)
    dimension = evaluate_bbox(componente)
    rectangle_boundary = rectangle(
        (dimension[0], dimension[1]), layer=layer, centered=True
    )
    rect_ref = componente << rectangle_boundary
    return rect_ref


def power_rails_placement(
    pdk,
    component: Component,
    width: float,
    alignment: int = 0,
    route_list: Optional[list] = None,
    specific_rail: Optional[list] = None,
    label: Optional[bool] = True,
    ports: Optional[bool] = True,
) -> Component:
    """power rails placemen
    Function that creates rails in the component to VDD, VSS or specified signal   
    args:
    pdk = pdk to use
    componente = component to which the rail is added
    alignment = rail's alignment, 0 horizontal and 1 vertical
    width = rail width
    route_list = list containing information about the ports that must be connected to the rails. [['port1', 'VSS'], ['port2', 'VDD'], ...]
    specific_rail = allows the creation of specific rails [['label', rail number]]
    label = add label to the rail
    ports = save rail's ports
    """

    if specific_rail != None:
        for info in specific_rail:
            if len(info) > 2:
                raise ValueError(
                    "Each component must be conformed by rail label and rail number (left to right)"
                )
    
    size_component = evaluate_bbox(component)
    
    if alignment == 0:
        rectangle_ref = rectangle(
            (size_component[0], width), layer=pdk.get_glayer("met4"), centered=True
        )
    elif alignment == 1:
        rectangle_ref = rectangle(
            (width, size_component[1]), layer=pdk.get_glayer("met5"), centered=True
        )
    else:
        raise ValueError("Alignment must be 0 or 1")
    
    temporal_component = Component()
   
    min_separation_met4 = pdk.get_grule("met4")["min_separation"]
    min_separation_met5 = pdk.get_grule("met5")["min_separation"]
    
    L = size_component[0] if alignment == 1 else size_component[1]
    
    W = width
    
    if alignment == 1:
        s_min = min_separation_met5 if W < min_separation_met5 else W / 2
    else:
        s_min = min_separation_met4 if W < min_separation_met4 else W / 2
    
    separation = W

    n = 1
    while True:
        s_n = (L - (2 * n + 1) * W) / (2 * n)
        if s_n < s_min:
            n -= 1
            break
        if s_n < separation:
            separation = s_n
        n += 1
    
    n_rectangles = n * 2 + 1
    space = separation + width
    carril = list()
    rail_list = list()
    prefix_list = list()
    #Espacio disponible de cada rail
    Available_space = dict()
    if specific_rail is not None:
        Available_space = {item[0]: [] for item in specific_rail}
    Available_space["VSS"] = []
    Available_space["VDD"] = []
    added_prefix = []
    for i in range(n_rectangles):
        carril.append(component << rectangle_ref)
        if alignment == 1:
            carril[-1].movex(pdk.snap_to_2xgrid(-size_component[0] / 2 + width / 2))
            carril[-1].movex(pdk.snap_to_2xgrid(space * i))
        else:
            carril[-1].movey(pdk.snap_to_2xgrid(-size_component[1] / 2 + width / 2))
            carril[-1].movey(pdk.snap_to_2xgrid(space * i))

        prefijo = None
        if specific_rail != None:
            for rail_info in specific_rail:
                if i + 1 == rail_info[1]:
                    prefijo = rail_info[0] + "_" + str(i + 1) + "_"
                    prefijo_label = rail_info[0]
                    rail_list.append(rail_info[0])
                    break
        if prefijo is None:
            if i % 2 == 0:
                prefijo = "VSS_" + str(i + 1) + "_"
                prefijo_label = 'VSS'
                rail_list.append("VSS")
            else:
                prefijo = "VDD_" + str(i + 1) + "_"
                prefijo_label = 'VDD'
                rail_list.append("VDD")
        prefix_list.append(prefijo)
        temporal_name_save = Component()
        temporal_name_save.add_ports(carril[-1].ports, prefix=prefijo)
        temporal_name_save = rename_ports_by_orientation(temporal_name_save)
        if ports:
            component.add_ports(temporal_name_save.ports)
        temporal_component.add_ports(temporal_name_save.ports)
        if alignment == 1 and label and prefijo_label not in added_prefix:
            pin_label_creation(pdk, prefijo[0:-1], prefijo_label, 'met5', component)
            added_prefix.append(prefijo_label)

        elif alignment == 0 and label and prefijo_label not in added_prefix:
            pin_label_creation(pdk, prefijo[0:-1], prefijo_label, 'met4', component)            
            added_prefix.append(prefijo_label)

    #ports = [
    #    name
    #    for name in component.ports
    #    if "Ref1_B_drain_T" in name or "Ref1_B_source_T" in name
    #]
    #print(ports)
    # Available spaces
    if route_list is not None:
        for i in range(len(rail_list)):
            if alignment == 1:
                Available_space[rail_list[i]].append(
                    [
                        temporal_component.ports[prefix_list[i] + "W"].center[0],
                        temporal_component.ports[prefix_list[i] + "E"].center[0],
                    ]
                )
            else:
                Available_space[rail_list[i]].append(
                    [
                        temporal_component.ports[prefix_list[i] + "S"].center[1],
                        temporal_component.ports[prefix_list[i] + "N"].center[1],
                    ]
                )

        # Via conection
        min_separation_via = pdk.get_grule("via4")["min_separation"] if alignment == 1 else pdk.get_grule("via3")["min_separation"]
        for route in route_list:
            if (len(route)) != 2:
                raise ValueError(
                    "Each route must be conformed by a port name and a rail name"
                )
            if route[1] not in Available_space:
                raise ValueError("The rail name must be in the specific rail list")
            
            port_E = route[0] + "E"
            port_W = route[0] + "W"
            port_N = route[0] + "N"
            port_S = route[0] + "S"
            #via creation
            if alignment == 1:
                via_ref = via_array(pdk, "met4", "met5", size=(width,component.ports[port_E].width))
            else:
                via_ref = via_array(pdk, "met3", "met4", size=(component.ports[port_N].width, width))
            size_via_ref = evaluate_bbox(via_ref)[0] if alignment == 1 else evaluate_bbox(via_ref)[1]
            separation = size_via_ref + min_separation_via
            # ports = [name for name in component.ports if 'Ref1_A_drain_T' in name]
            if alignment == 1:
                range_ports_available = [
                    component.ports[port_W].center[0],
                    component.ports[port_E].center[0],
                ]
            else:
                range_ports_available = [
                    component.ports[port_S].center[1],
                    component.ports[port_N].center[1],
                ]

            # Espacio disponible en la ruta donde se van a agregar las vias
            space_available_route = abs(range_ports_available[1] - range_ports_available[0])
            if space_available_route < separation:
                raise ValueError("There is not enough space to add the via")
            vias = list()
            connected = False
            for i in range(len(Available_space[route[1]])):
                if alignment == 1:
                    movement_x = Available_space[route[1]][i][0] + size_via_ref/2   #centro horizontal de la ruta
                    movement_y = (component.ports[port_E].center[1])                #base de cada rail que se conecta con la ruta
                    if range_ports_available[0] < movement_x < range_ports_available[1] or range_ports_available[1] < movement_x < range_ports_available[0]:
                        vias.append(component << via_ref)
                        vias[-1].movex(movement_x).movey(movement_y)
                        connected = True
                else:
                    movement_x = (component.ports[port_S].center[0])                #centro vertical de la ruta
                    movement_y = Available_space[route[1]][i][0] + size_via_ref/2   #base de cada rail que se conecta con la ruta
                    if range_ports_available[0] < movement_y < range_ports_available[1] or range_ports_available[1] < movement_y < range_ports_available[0]:
                        vias.append(component << via_ref)
                        vias[-1].movex(movement_x).movey(movement_y)
                        connected = True
            if connected == False:
                print(route[0] + ' was not connected')

# Bias Ciruit
---
The Component_Biasing function constructs and organizes the core of a biasing circuit from six interdigitated transistor arrays (M1–M6). For this purpose, it instantiates each block using interdigitated layout generators, computes horizontal offsets based on device widths to comply with design-rule spacing requirements, and performs the internal routing of sources, drains, gates, and bulk regions across different metal layers. Finally, it centers the component, defines the bias input and output ports, and returns a fully integrated biasing block ready for hierarchical design integration.

The Biasing_generator function extends the biasing core by adding a seventh cascode block (M7) using interdigitado_cascode_placement_Onchip, which is positioned and aligned with respect to the previously generated core structure.

In [7]:
def Component_Biasing(pdk: MappedPDK,
                        devices_info, 
                        arrays_info,
                        width_route: float = None,
                        offset_drc: float = 0) -> Component:
    
    # Width configuration
    if width_route == None or width_route == 0:
        separation_interdigitado = 0
        width_horizontal = evaluate_bbox(via_stack(pdk,'met2','met3'))[1]
    else:
        separation_interdigitado = width_route
        width_horizontal = width_route
    # min separations
    min_separation_met4 = pdk.get_grule('met4')['min_separation']
    min_separation_met3 = pdk.get_grule('met3')['min_separation']
    min_separation_met2 = pdk.get_grule('met2')['min_separation']
    min_separation_nwell = pdk.get_grule('nwell')['min_separation']
    # diff size offset
    offsetM1M2 = round((abs((devices_info[0]['width'] - devices_info[1]['width']))* 3/2 )/2, 2)
    offsetM1 = offsetM1M2 if devices_info[1]['width'] - 0.02 > devices_info[0]['width'] else 0

    offsetM2M3 = round((abs((devices_info[2]['width'] - devices_info[1]['width']))* 3/2 + 0.12)/2, 2)
    offsetM2 = offsetM2M3 if devices_info[2]['width'] - 0.02 > devices_info[1]['width'] else 0
    offsetM3 = offsetM2M3 if devices_info[1]['width'] - 0.02 > devices_info[2]['width'] else 0

    offsetM4M6 = round((abs((devices_info[3]['width'] - devices_info[5]['width']))* 3/2 + 0.12)/2, 2)
    offsetM4 = offsetM4M6 if devices_info[5]['width'] - 0.02 > devices_info[3]['width'] else 0
    offsetM6 = offsetM4M6 if devices_info[3]['width'] - 0.02 > devices_info[5]['width'] else 0
    # Create the component
    biasing = Component()

    M1_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, False), deviceA_and_B=devices_info[0]['type'],
                                             width=devices_info[0]['width'], length=devices_info[0]['length'], fingers=devices_info[0]['fingers'], 
                                             with_dummy=True, array=arrays_info[0], with_tie=True, with_lvt_layer=devices_info[0]['lvt'], 
                                             output_separation=(separation_interdigitado + offsetM1, separation_interdigitado), routed = True)
    
    M2_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, False), deviceA_and_B=devices_info[1]['type'],
                                             width=devices_info[1]['width'], length=devices_info[1]['length'], fingers=devices_info[1]['fingers'], 
                                             with_dummy=True, array=arrays_info[1], with_tie=True, with_lvt_layer=devices_info[1]['lvt'], 
                                             output_separation=(separation_interdigitado + offsetM2, separation_interdigitado), routed = True)

    M3_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, True), deviceA_and_B=devices_info[2]['type'],
                                             width=devices_info[2]['width'], length=devices_info[2]['length'], fingers=devices_info[2]['fingers'], 
                                             with_dummy=True, array=arrays_info[2], with_tie=True, with_lvt_layer=devices_info[2]['lvt'], 
                                             output_separation=(separation_interdigitado + offsetM3, separation_interdigitado), routed = True)
    M4_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, False), deviceA_and_B=devices_info[3]['type'],
                                             width=devices_info[3]['width'], length=devices_info[3]['length'], fingers=devices_info[3]['fingers'], 
                                             with_dummy=True, array=arrays_info[3], with_tie=True, with_lvt_layer=devices_info[3]['lvt'], 
                                             output_separation=(separation_interdigitado + offsetM4, separation_interdigitado), routed = True)

    M5_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, False), deviceA_and_B=devices_info[4]['type'],
                                             width=devices_info[4]['width'], length=devices_info[4]['length'], fingers=devices_info[4]['fingers'], 
                                             with_dummy=True, array=arrays_info[4], with_tie=True, with_lvt_layer=devices_info[4]['lvt'], 
                                             output_separation=(separation_interdigitado, separation_interdigitado), gate_common=False, routed = False)
    
    M6_ref = interdigitado_placement_Onchip(pdk, output='via', common_route=(False, False), deviceA_and_B=devices_info[5]['type'],
                                             width=devices_info[5]['width'], length=devices_info[5]['length'], fingers=devices_info[5]['fingers'], 
                                             with_dummy=True, array=arrays_info[5], with_tie=True, with_lvt_layer=devices_info[5]['lvt'], 
                                             output_separation=(separation_interdigitado + offsetM6, separation_interdigitado), routed = True)
    
    # Sizes referencias
    size_M1 = evaluate_bbox(M1_ref)
    size_M2 = evaluate_bbox(M2_ref)
    size_M3 = evaluate_bbox(M3_ref)
    size_M4 = evaluate_bbox(M4_ref)
    size_M5 = evaluate_bbox(M5_ref)
    size_M6 = evaluate_bbox(M6_ref)

    direccion = 0   #0 x, 1 y
    M2_x = pdk.snap_to_2xgrid((size_M1[direccion]+size_M2[direccion])/2 + min_separation_nwell + 0.1)    
    M3_x = pdk.snap_to_2xgrid(M2_x + (size_M2[direccion]+size_M3[direccion])/2 + min_separation_nwell + 0.1)
    M6_x = pdk.snap_to_2xgrid(M3_x + (size_M3[direccion]+size_M6[direccion])/2 + min_separation_nwell + 0.1)
    M4_x = pdk.snap_to_2xgrid(M6_x + (size_M6[direccion]+size_M4[direccion])/2 + min_separation_nwell + 0.1)
    M5_x = pdk.snap_to_2xgrid(M4_x + (size_M4[direccion]+size_M5[direccion])/2 + min_separation_nwell + 0.1)

    # Add components
    M1 = biasing << M1_ref
    M2 = biasing << M2_ref
    M3 = biasing << M3_ref
    M4 = biasing << M4_ref
    M5 = biasing << M5_ref
    M6 = biasing << M6_ref

    # Move components
    M2.movex(M2_x).movey(offset_drc)
    M3.movex(M3_x).movey(offset_drc)
    M4.movex(M4_x).movey(offset_drc)
    M5.movex(M5_x).movey(-min_separation_met2 + offset_drc)
    M6.movex(M6_x).movey(offset_drc)

    M2.movex(offset_drc)
    M3.movex(offset_drc)
    M4.movex(offset_drc)
    M5.movex(offset_drc)
    M6.movex(offset_drc)

    #Auxiliar vias
    via_3_4 = via_stack(pdk, 'met3', 'met4')
    #Reference ports
    index_list = []
    for array in arrays_info:
        indices = {}
        for i, val in enumerate(array[0]):
            if val not in indices:  # primera vez que aparece
                indices[val] = [i, i]
            else:  # actualizar última aparición
                indices[val][1] = i
        index_list.append(indices)

    # Routing
    biasing << straight_route(pdk, M3.ports['source_1_'+str(arrays_info[2][0][0])+'_0_W'], M3.ports['source_'+str(len(arrays_info[2][0]))+'_'+str(arrays_info[2][0][-1])+'_0_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met2', width = width_horizontal)
    biasing << straight_route(pdk, M5.ports['drain_'+str(index_list[4][1][0]+1)+'_1_0_W'], M5.ports['drain_'+str(index_list[4][1][1]+1)+'_1_0_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met2', width = width_horizontal)
    biasing << straight_route(pdk, M5.ports['source_'+str(index_list[4][1][0]+1)+'_1_0_W'], M5.ports['source_'+str(index_list[4][1][1]+1)+'_1_0_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met2', width = width_horizontal)
    biasing << straight_route(pdk, M5.ports['source_'+str(index_list[4][2][0]+1)+'_2_0_W'], M5.ports['source_'+str(index_list[4][2][1]+1)+'_2_0_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met2', width = width_horizontal)

    #gates
    biasing << straight_route(pdk, M5.ports[str(index_list[4][1][0]+1)+'_1_gate_W'], M5.ports[str(index_list[4][1][1]+1)+'_1_gate_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met3')
    biasing << straight_route(pdk, M5.ports[str(index_list[4][2][0]+1)+'_2_gate_W'], M5.ports[str(index_list[4][2][1]+1)+'_2_gate_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met3')
    
    #Internal routing
    for i in range(len(arrays_info[0][0])):
        if arrays_info[0][0][i] == 2:
            biasing << straight_route(pdk, M1.ports['source_'+str(i+1)+'_'+str(arrays_info[0][0][i])+'_0_N'], M1.ports['bulk_down_S'], via2_alignment_layer='met2')  
    biasing << L_route(pdk, M1.ports['source_'+str(index_list[0][1][0]+1)+'_1_0_N'], M1.ports['drain_'+str(index_list[0][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)

    for i in range(len(arrays_info[1][0])):
        if arrays_info[1][0][i] == 1:
            biasing << straight_route(pdk, M2.ports['source_'+str(i+1)+'_'+str(arrays_info[1][0][i])+'_0_N'], M2.ports['bulk_down_S'], via2_alignment_layer='met2') 

    biasing << L_route(pdk, M2.ports['source_'+str(index_list[1][2][0]+1)+'_2_0_N'], M2.ports['drain_'+str(index_list[0][1][0]+1)+'_1_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M2.ports['gate1_N'], M2.ports['drain_'+str(index_list[1][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M2.ports['gate2_N'], M2.ports['drain_'+str(index_list[1][2][0]+1)+'_2_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)


    for i in range(len(arrays_info[2][0])):
        biasing << straight_route(pdk, M3.ports['source_'+str(i+1)+'_'+str(arrays_info[2][0][i])+'_0_N'], M3.ports['bulk_down_S'], via2_alignment_layer='met2') 
    
    biasing << L_route(pdk, M3.ports['gate1_N'], M3.ports['drain_'+str(index_list[2][1][0]+1)+'_1_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M3.ports['gate2_N'], M3.ports['drain_'+str(index_list[2][1][0]+1)+'_1_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)    

    for i in range(len(arrays_info[3][0])):
        if arrays_info[3][0][i] == 1:
            #bulk
            biasing << straight_route(pdk, M4.ports['source_'+str(i+1)+'_'+str(arrays_info[3][0][i])+'_0_N'], M4.ports['bulk_down_S'], via2_alignment_layer='met2')
            #
            biasing << L_route(pdk, M4.ports['drain_'+str(i+1)+'_'+str(arrays_info[3][0][i])+'_0_S'], M4.ports['source_'+str(index_list[3][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    
    biasing << L_route(pdk, M4.ports['gate1_N'], M4.ports['drain_'+str(index_list[3][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M4.ports['gate2_N'], M4.ports['drain_'+str(index_list[3][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)

    for i in range(len(arrays_info[4][0])):
        if arrays_info[4][0][i] == 1:
            biasing << straight_route(pdk, M5.ports['source_'+str(i+1)+'_'+str(arrays_info[4][0][i])+'_0_N'], M5.ports['bulk_down_S'], via2_alignment_layer='met2') 
            biasing << L_route(pdk, M5.ports['drain_'+str(i+1)+'_'+str(arrays_info[4][0][i])+'_0_S'], M5.ports['source_'+str(index_list[4][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
        if arrays_info[4][0][i] == 2:
            biasing << L_route(pdk, M5.ports['drain_'+str(i+1)+'_'+str(arrays_info[4][0][i])+'_0_S'], M5.ports[str(index_list[4][1][0]+1)+'_1_gate_E'], hglayer='met2', vglayer='met3')
    
    #External conections
    biasing << L_route(pdk, M1.ports['source_'+str(index_list[0][2][1]+1)+'_2_0_W'], M2.ports['source_'+str(index_list[1][1][0]+1)+'_1_0_N'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    extension_m1m3 = M1.ports['drain_'+str(index_list[0][2][0]+1)+'_2_0_N'].center[1] - M1.ports['drain_'+str(index_list[0][1][0]+1)+'_1_0_N'].center[1] + width_horizontal
    biasing << c_route(pdk, M1.ports['drain_'+str(index_list[0][1][0]+1)+'_1_0_N'], M3.ports['drain_'+str(index_list[2][1][0]+1)+'_1_0_N'], cglayer='met2', cwidth=width_horizontal, extension=extension_m1m3)
    biasing << straight_route(pdk, M2.ports['drain_'+str(index_list[1][2][0]+1)+'_2_0_W'], M3.ports['drain_'+str(index_list[2][1][0]+1)+'_1_0_E'], glayer1='met2', glayer2='met2', via1_alignment_layer='met3', width = width_horizontal)
    biasing << L_route(pdk, M6.ports['gate1_N'], M2.ports['drain_'+str(index_list[1][2][0]+1)+'_2_0_E'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M6.ports['drain_'+str(index_list[5][1][0]+1)+'_1_0_N'], M3.ports['drain_'+str(index_list[2][3][0]+1)+'_3_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, M5.ports[str(index_list[4][2][0]+1)+'_2_gate_E'], M4.ports['gate2_N'], hglayer='met2', vglayer='met3')
    biasing << straight_route(pdk, M6.ports['drain_'+str(index_list[5][2][0]+1)+'_2_0_W'], M4.ports['gate1_E'], glayer1='met2', glayer2='met2' ,width = width_horizontal)

    for i in range(len(arrays_info[4][0])):
        if arrays_info[4][0][i] == 2:
            biasing << c_route(pdk, M6.ports['drain_'+str(index_list[5][3][0]+1)+'_3_0_N'], M5.ports['drain_'+str(i+1)+'_'+str(arrays_info[4][0][i])+'_0_N'], cglayer='met2', cwidth=width_horizontal, extension=2*min_separation_met2)

    #saving ports
    biasing.add_ports(M1.ports, prefix='M1_')
    biasing.add_ports(M2.ports, prefix='M2_')
    biasing.add_ports(M3.ports, prefix='M3_')
    biasing.add_ports(M4.ports, prefix='M4_')
    biasing.add_ports(M5.ports, prefix='M5_')
    biasing.add_ports(M6.ports, prefix='M6_')

    # Centered and boundary
    biasing_centered = center_component_with_ports(pdk, biasing)

    boundary_dim = evaluate_bbox(biasing_centered)
    
    #Input/Output rectangle
    rectangle_ref = rectangle((0.5,0.5), layer=pdk.get_glayer('met2'), centered=True)

    #Inputs
    Vref = biasing_centered << rectangle_ref
    Vref.movey(pdk.snap_to_2xgrid(biasing_centered.ports['M1_gate1_W'].center[1]))
    Vref.movex(pdk.snap_to_2xgrid(-boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]-min_separation_met3))
    biasing_centered << straight_route(pdk, Vref.ports['e1'], biasing_centered.ports['M1_gate1_E'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(Vref.get_ports_list(), prefix='V_REF_P_')

    #Outputs
    VbiasP1 = biasing_centered << rectangle_ref
    VbiasP1.movey(pdk.snap_to_2xgrid(-boundary_dim[1]/2-evaluate_bbox(rectangle_ref)[1]-min_separation_met2))
    VbiasP1.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << L_route(pdk, VbiasP1.ports['e3'], biasing_centered.ports['M3_gate1_S'], hglayer='met2', vglayer='met3')
    biasing_centered << L_route(pdk, VbiasP1.ports['e3'], biasing_centered.ports['M3_gate2_S'], hglayer='met2', vglayer='met3')
    biasing_centered.add_ports(VbiasP1.ports, prefix='V_BIASP1_P_')

    VbiasP2 = biasing_centered << rectangle_ref
    VbiasP2.movey(pdk.snap_to_2xgrid(biasing_centered.ports['M5_'+str(index_list[4][2][0]+1)+'_2_gate_W'].center[1]))
    VbiasP2.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << straight_route(pdk, VbiasP2.ports['e1'], biasing_centered.ports['M5_'+str(index_list[4][2][1]+1)+'_2_gate_W'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(VbiasP2.ports, prefix='V_BIASP2_P_')

    VbiasN2 = biasing_centered << rectangle_ref
    VbiasN2.movey(pdk.snap_to_2xgrid(-boundary_dim[1]/2-2*evaluate_bbox(rectangle_ref)[1]-2*min_separation_met2))
    VbiasN2.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << L_route(pdk, VbiasN2.ports['e3'], biasing_centered.ports['M6_gate1_S'], hglayer='met2', vglayer='met3')
    biasing_centered << L_route(pdk, VbiasN2.ports['e3'], biasing_centered.ports['M6_gate2_S'], hglayer='met2', vglayer='met3')
    biasing_centered.add_ports(VbiasN2.ports, prefix='V_BIASN2_P_')

    rename_ports_by_orientation(biasing_centered)
    
    component = center_component_with_ports(pdk, biasing_centered)
   
    return component

def Biasing_generator(pdk, 
                      devices_info, 
                      arrays_info, 
                      width_route: float = None,
                      offset_drc: float = 0.0) -> Component:

    # Width configuration
    if width_route == None or width_route == 0:
        separation_interdigitado = 0
        width_horizontal = evaluate_bbox(via_stack(pdk,'met2','met3'))[1]
    else:
        separation_interdigitado = width_route
        width_horizontal = width_route
    # min separations
    min_separation_met4 = pdk.get_grule('met4')['min_separation']
    min_separation_met3 = pdk.get_grule('met3')['min_separation']
    min_separation_met2 = pdk.get_grule('met2')['min_separation']
    # Create the component
    biasing = Component()

    #Reference ports
    index_list = []
    for array in arrays_info:
        indices = {}
        for i, val in enumerate(array[0]):
            if val not in indices:  # primera vez que aparece
                indices[val] = [i, i]
            else:  # actualizar última aparición
                indices[val][1] = i
        index_list.append(indices)

    top_components_ref = Component_Biasing(pdk, devices_info, arrays_info, width_route, offset_drc)
    M7_ref = interdigitado_cascode_placement_Onchip(pdk, output='via', common_route=(False, True), output_separation=(separation_interdigitado, width_route),
                                                    deviceA_and_B=devices_info[6]['type'], width=devices_info[6]['width'], length=devices_info[6]['length'], 
                                                    fingers=devices_info[6]['fingers'], with_dummy=devices_info[6]['with_dummy'], array=arrays_info[6], 
                                                    with_tie=devices_info[6]['with_tie'], with_lvt_layer=devices_info[6]['lvt'], routed=True)
    # Sizes referencias
    size_top = evaluate_bbox(top_components_ref)
    size_M7 = evaluate_bbox(M7_ref)

    # Add components
    top = biasing << top_components_ref
    M7 = biasing << M7_ref
    
    # Movement
    M7_y = pdk.snap_to_2xgrid((size_top[1]+size_M7[1])/2 + min_separation_met4 + separation_interdigitado)
    # Horizontal alignement
    port1_x = top.ports['M6_source_'+str(index_list[5][1][0]+1)+'_1_0_S'].center[0]
    port2_x = top.ports['M6_source_'+str(index_list[5][2][0]+1)+'_2_0_S'].center[0]
    port3_x = top.ports['M6_source_'+str(index_list[5][3][0]+1)+'_3_0_S'].center[0]
    top_ports_x = [port1_x, port2_x, port3_x]
        #conection port
    ports1 = list()
    ports2 = list()
    ports3 = list()
    for i in range(len(arrays_info[6][0])):
        if arrays_info[6][0][i] == 1:
            ports1.append(M7.ports['drain_'+str(i+1)+'_1_0_N'].center[0])
        elif arrays_info[6][0][i] == 2:
            ports2.append(M7.ports['drain_'+str(i+1)+'_2_0_N'].center[0])
        elif arrays_info[6][0][i] == 3:
            ports3.append(M7.ports['drain_'+str(i+1)+'_3_0_N'].center[0])
    m7_ports_x = [ports1, ports2, ports3]
    x_offset = 0
    moved = False
    for i in range(3):
        if moved:
            break
        range_av = [top_ports_x[i]-0.25-min_separation_met3, top_ports_x[i]+0.25+min_separation_met3]
        for port_list in range(len(m7_ports_x)):
            if moved:
                break
            elif i <= port_list:
                for j in range(len(m7_ports_x[port_list])):
                    if range_av[0] < m7_ports_x[port_list][j] < range_av[1]:
                        x_offset += 0.5 + min_separation_met3
                        moved = True
                        break
        
    
    print(x_offset)
                
    #Move components
    M7.movey(-M7_y)
    M7.movey(offset_drc)
    M7.movex(x_offset + offset_drc)

    #Auxiliar vias
    via_3_4 = via_stack(pdk, 'met3', 'met4')    

    #Routing
    #Internal routing
    #M7
    for i in range(len(arrays_info[6][0])):
        #bulk
        biasing << straight_route(pdk, M7.ports['source_'+str(i+1)+'_'+str(arrays_info[6][0][i])+'_0_N'], M7.ports['bulk_down_S'], via2_alignment_layer='met2') 
        #
    biasing << straight_route(pdk, M7.ports['gate_1_l_S'], M7.ports['gate_2_l_N'], glayer1 = 'met3', glayer2 = 'met3')
    biasing << straight_route(pdk, M7.ports['gate_1_r_S'], M7.ports['gate_2_r_N'], glayer1 = 'met3', glayer2 = 'met3')
    
    #External routing
    top.ports['M6_bulk_down_N'].layer =  pdk.get_glayer('met1')
    biasing << straight_route(pdk, top.ports['M6_bulk_down_N'], M7.ports['bulk_up_E'], width=1, glayer1 = 'met1', glayer2='met1')

    biasing << L_route(pdk, top.ports['M6_source_'+str(index_list[5][1][0]+1)+'_1_0_N'], M7.ports['drain_'+str(index_list[6][1][0]+1)+'_1_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, top.ports['M6_source_'+str(index_list[5][2][0]+1)+'_2_0_N'], M7.ports['drain_'+str(index_list[6][2][0]+1)+'_2_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing << L_route(pdk, top.ports['M6_source_'+str(index_list[5][3][0]+1)+'_3_0_N'], M7.ports['drain_'+str(index_list[6][3][0]+1)+'_3_0_W'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)

    #auxiliar via
    via_2_3_ref = via_stack(pdk, 'met2', 'met3')
    position_top_component = top.bbox[1][1] + width_horizontal
    position_left_component = round(-evaluate_bbox(biasing)[0]/2 - evaluate_bbox(via_2_3_ref)[0]/2 - width_horizontal/2, 2)
    position_right_component = round(evaluate_bbox(biasing)[0]/2 + evaluate_bbox(via_2_3_ref)[0]/2 + width_horizontal/2, 2)
    via_M3M7_left = biasing << via_2_3_ref
    via_M3M7_left.movex(position_left_component-min_separation_met3)
    via_M3M7_left.movey(position_top_component + min_separation_met2)
    biasing << L_route(pdk, top.ports['M3_drain_'+str(index_list[2][3][0]+1)+'_3_0_S'], via_M3M7_left.ports['bottom_met_W'], vwidth = width_horizontal)
    biasing << L_route(pdk, via_M3M7_left.ports['top_met_N'], M7.ports['gate_1_l_E'], hglayer = 'met2', vglayer='met3', hwidth = width_horizontal, vwidth=width_horizontal)
    biasing << L_route(pdk, via_M3M7_left.ports['top_met_N'], M7.ports['gate_2_l_E'], hglayer = 'met2', vglayer='met3', hwidth = width_horizontal, vwidth=width_horizontal)

    via_M3M7_right = biasing << via_2_3_ref
    via_M3M7_right.movex(position_right_component+min_separation_met3)
    via_M3M7_right.movey(position_top_component + min_separation_met2)
    biasing << L_route(pdk, top.ports['M3_drain_'+str(index_list[2][3][0]+1)+'_3_0_S'], via_M3M7_right.ports['bottom_met_E'], vwidth = width_horizontal)
    biasing << L_route(pdk, via_M3M7_right.ports['top_met_N'], M7.ports['gate_1_r_W'], hglayer = 'met2', vglayer='met3', hwidth = width_horizontal, vwidth=width_horizontal)
    biasing << L_route(pdk, via_M3M7_right.ports['top_met_N'], M7.ports['gate_2_r_W'], hglayer = 'met2', vglayer='met3', hwidth = width_horizontal, vwidth=width_horizontal)
    
    #Add ports to component
    biasing.add_ports(top.ports)
    biasing.add_ports(M7.ports, prefix='M7_')

    # Centered
    biasing_centered = center_component_with_ports(pdk, biasing)

    boundary_dim = evaluate_bbox(biasing_centered)

    #Input/Output rectangle
    rectangle_ref = rectangle((0.5,0.5), layer=pdk.get_glayer('met2'), centered=True)

    #Inputs
    Vref = biasing_centered << rectangle_ref
    Vref.movey(pdk.snap_to_2xgrid(biasing_centered.ports['V_REF_P_W'].center[1]))
    Vref.movex(pdk.snap_to_2xgrid(-boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]-min_separation_met3))
    biasing_centered << straight_route(pdk, Vref.ports['e1'], biasing_centered.ports['V_REF_P_E'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(Vref.get_ports_list(), prefix='V_REF_')

    #Outputs
    VbiasP1 = biasing_centered << rectangle_ref
    VbiasP1.movey(pdk.snap_to_2xgrid(biasing_centered.ports['V_BIASP1_P_W'].center[1]))
    VbiasP1.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << straight_route(pdk, VbiasP1.ports['e1'], biasing_centered.ports['V_BIASP1_P_W'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(VbiasP1.ports, prefix='V_BIASP1_')

    VbiasP2 = biasing_centered << rectangle_ref
    VbiasP2.movey(pdk.snap_to_2xgrid(biasing_centered.ports['V_BIASP2_P_W'].center[1]))
    VbiasP2.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << straight_route(pdk, VbiasP2.ports['e1'], biasing_centered.ports['V_BIASP2_P_W'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(VbiasP2.ports, prefix='V_BIASP2_')

    VbiasN1 = biasing_centered << rectangle_ref
    VbiasN1.movey(pdk.snap_to_2xgrid((biasing_centered.ports['M7_gate_2_r_W'].center[1]+biasing_centered.ports['M7_gate_1_r_W'].center[1])/2))
    VbiasN1.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << L_route(pdk, VbiasN1.ports['e3'], biasing_centered.ports['M7_gate_2_r_S'], hglayer='met2', vglayer='met3', vwidth = width_horizontal)
    biasing_centered.add_ports(VbiasN1.ports, prefix='V_BIASN1_')

    VbiasN2 = biasing_centered << rectangle_ref
    VbiasN2.movey(pdk.snap_to_2xgrid(biasing_centered.ports['V_BIASN2_P_W'].center[1]))
    VbiasN2.movex(pdk.snap_to_2xgrid(boundary_dim[0]/2+evaluate_bbox(rectangle_ref)[0]+min_separation_met3))
    biasing_centered << straight_route(pdk, VbiasN2.ports['e1'], biasing_centered.ports['V_BIASN2_P_W'], glayer1='met2', glayer2='met2')
    biasing_centered.add_ports(VbiasN2.ports, prefix='V_BIASN2_')

    #Centered and boundary
    biasing_centered = center_component_with_ports(pdk, biasing_centered)
    rename_ports_by_orientation(biasing_centered)

    #Rails
    route_list_hor = [['M1_source_'+str(index_list[0][2][0]+1)+'_2_0_route_','VSS'], ['M2_source_'+str(index_list[1][1][0]+1)+'_1_0_route_', 'VSS']]
    #VDD
    for i in range(len(arrays_info[2][0])):
        route = []
        route.append('M3_source_'+str(i+1)+'_'+str(arrays_info[2][0][i])+'_0_route_')
        route.append('VDD')
        route_list_hor.append(route)
    for i in range(len(arrays_info[3][0])):
        route = []
        if arrays_info[3][0][i] == 1:
            route.append('M4_source_'+str(i+1)+'_'+str(arrays_info[3][0][i])+'_0_route_')
            route.append('VDD')
            route_list_hor.append(route)
    for i in range(len(arrays_info[4][0])):
        route = []
        if arrays_info[4][0][i] == 1:
            route.append('M5_source_'+str(i+1)+'_'+str(arrays_info[4][0][i])+'_0_route_')
            route.append('VDD')
            route_list_hor.append(route)
    #VSS        
    for i in range(len(arrays_info[6][0])):
        route = []
        route.append('M7_source_'+str(i+1)+'_'+str(arrays_info[6][0][i])+'_0_route_')
        route.append('VSS')
        route_list_hor.append(route)
    
    route_list_ver = []

    #Save ports

    component = Component()
    component << biasing_centered

    filtrar_puertos(biasing_centered, component, 'V_REF_', 'VREF_', True)
    filtrar_puertos(biasing_centered, component, 'V_BIASN1_', 'VBIASN1_', True)
    filtrar_puertos(biasing_centered, component, 'V_BIASN2_', 'VBIASN2_', True)
    filtrar_puertos(biasing_centered, component, 'V_BIASP1_', 'VBIASP1_', True)
    filtrar_puertos(biasing_centered, component, 'V_BIASP2_', 'VBIASP2_', True)
    for route in route_list_hor:
        filtrar_puertos(biasing_centered, component, route[0])

    return component_snap_to_grid(component), route_list_hor

def generator_bias():
    # Information of the transistors
    array_m1 = [[1,2]]
    array_m2 = [[1,2]]
    array_m3 = [[2,1,3]]
    array_m4 = [[1,2]]
    array_m5 = [[2,1]]
    array_m6 = [[1,2,3]]
    array_m7 = [[3,3,2,2,1,1,1,1,2,2,3,3,3,3,2,2,1,1,1,1,2,2,3,3,3,3,2,2,1,1,1,1,2,2,3,3,3,3,2,2,1,1,1,1,2,2,3,3]]

    dum_m1 = (len(array_m1[0])+2)*2 + 2
    dum_m2 = (len(array_m2[0])+2)*2 + 2
    dum_m3 = (len(array_m3[0])+2)*2 + 2
    dum_m4 = (len(array_m4[0])+2)*2 + 2
    dum_m5 = (len(array_m5[0])+2)*2 + 2
    dum_m6 = (len(array_m6[0])+2)*2 + 2
    dum_m7 = (len(array_m7[0])+2)*2 + 4
    
    print(f'dummys M1 = {dum_m1}')
    print(f'dummys M2 = {dum_m2}')
    print(f'dummys M3 = {dum_m3}')
    print(f'dummys M4 = {dum_m4}')
    print(f'dummys M5 = {dum_m5}')
    print(f'dummys M6 = {dum_m6}')
    print(f'dummys M7 = {dum_m7}')

    devices_info_m1 = {'type':'nfet', 'name':'M1', 'width':1.00, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m2 = {'type':'nfet', 'name':'M1', 'width':0.50, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m3 = {'type':'pfet', 'name':'M1', 'width':1.00, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m4 = {'type':'pfet', 'name':'M1', 'width':1.00, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m5 = {'type':'pfet', 'name':'M1', 'width':1.00, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m6 = {'type':'nfet', 'name':'M1', 'width':0.50, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    devices_info_m7 = {'type':'nfet', 'name':'M1', 'width':2.00, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}

    devices_info = [devices_info_m1, devices_info_m2, devices_info_m3, devices_info_m4, devices_info_m5, devices_info_m6, devices_info_m7]
    arrays_info = [array_m1, array_m2, array_m3, array_m4, array_m5, array_m6, array_m7]

    bias_core, rails_route_list = Biasing_generator(gf180, devices_info, arrays_info, width_route=1, offset_drc = 0.00)
    # Display the current mirror layout at Klayout:
    #bias_core.name = "error_amplifier_N_input_bias"
    #bias_core.write_gds("error_amplifier_N_input_bias_pcells.gds")
    #bias_core.show()
    #display_component(bias_core, "error_amplifier_N_input_bias_pcells")
    return bias_core, rails_route_list

#if __name__ == "__main__":
    # If called directly call main function
    # generator_bias()

The following code constitutes a library for the automatic generation of layouts corresponding to basic analog circuit topologies. Based on the technological information provided by the PDK, the device parameters, and matrices defining the physical organization, the code constructs high-level circuit blocks such as current mirrors, individual transistors (with or without body effect), diode-connected transistors, current sources, differential pairs, cascode structures, and MOS capacitors (MOSCAPs).

Each block is generated with its internal routing (source, drain, gate, and bulk), standardized ports, and, optionally, pins and labels to facilitate integration into higher-level schematics. In this way, the set of functions provides a collection of reusable and parameterizable primitives, enabling the systematic instantiation of fundamental circuit topologies, ready to be connected and combined in more complex analog designs.

In [8]:
def mirror(pdk: MappedPDK, devices_info, matrix, with_pin: int = 0) -> Component:
    mirror = Component()
    """"
    pdk = pdk to use
    devices_info = the devices to place, usually formed as an array with all the information
    matrix = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose

    Mirror primitive, can be used in its NMOS version or PMOS 
    """
    # Matrix placement

    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'])

    matrix = mirror << config
    mirror.add_ports(matrix.get_ports_list())
    
    # Evaluate the dimensions
    ################################
    size_component = evaluate_bbox(matrix)

    # Routing 
    #####################

    # Source to Source (A -> B)
    route_Src = mirror << L_route(pdk, matrix.ports['A_source_N'], matrix.ports['B_source_E'])

    # Gate to Drain (A -> A (B))
    route_gate_drain_A = mirror << L_route(pdk, matrix.ports['A_gate_S'], matrix.ports['A_drain_W'])

    # Bulk routing (Neglecting Body Effect)
    route_bulk_1 = mirror << straight_route(pdk, matrix.ports['A_source_N'], matrix.ports['bulk_down_S'], glayer1='met3', glayer2='met3')
    route_bulk_2 = mirror << straight_route(pdk, matrix.ports['B_source_N'], matrix.ports['bulk_down_S'], glayer1='met3', glayer2='met3')

    ## External o Internal device

    if with_pin == 1:
        # Pin creation
        pin_label_creation('A_drain', 'V_REF', 'met3', mirror)
        pin_label_creation('B_drain', 'V_OUT', 'met3', mirror)
        pin_label_creation('B_source', 'VS', 'met3', mirror)
        pin_label_creation('A_gate', 'VB', 'met3', mirror)

    

    component = Component()
    component << mirror

    filtrar_puertos(mirror, component, 'A_drain_', 'V_REF_')
    filtrar_puertos(mirror, component, 'B_drain_', 'V_OUT_')
    filtrar_puertos(mirror, component, 'B_source_', 'VS_')
    filtrar_puertos(mirror, component, 'A_gate_', 'VB_')

    return component

### Single transistor primitive ###

def transistor(pdk, devices_info, matrix, with_pin: int = 0, with_b_effect: int = 0, true_size: int = 0) -> Component:
    transistor = Component()
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    matrix = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose
    with_b_effect = Allows to have or not to have a bulk port
    true_size = saves extra ports to rail function, these ports include all the metal to add vias

    Transistor primitive, can be used in its NMOS version or PMOS, it already neglects the body effect
    """
    #Matrix placement

    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'], full_output_size = true_size)

    matrix = transistor << config
    transistor.add_ports(matrix.get_ports_list())

    # Evaluate the dimensions
    ################################
    size_component = evaluate_bbox(matrix)

    # Routing 
    #####################

    if with_b_effect == 0:

        # Bulk routing (Neglecting Body Effect)
        via_ref = via_stack(pdk, 'met2', 'met3')

        via_bulk = transistor << via_ref
        via_bulk.movex(matrix.ports['A_source_N'].center[0]).movey(matrix.ports['bulk_down_E'].center[1])
        
        route_bulk_1 = transistor << straight_route(pdk, matrix.ports['A_source_S'], via_bulk.ports['top_met_N'])

        ## External o Internal device

        if with_pin == 1:
            
            #Pin creation
            pin_label_creation('A_drain', 'VD', 'met3', transistor)
            pin_label_creation('A_gate', 'VG', 'met3', transistor)
            pin_label_creation('A_source', 'VS', 'met3', transistor)

    

        component = Component()
        component << transistor

        filtrar_puertos(transistor, component, 'A_drain_', 'VD_')
        filtrar_puertos(transistor, component, 'A_gate_', 'VG_')
        filtrar_puertos(transistor, component, 'A_source_', 'VS_')
        filtrar_puertos(transistor, component, 'bulk_down_', 'VBC_D_')
        filtrar_puertos(transistor, component, 'bulk_up_', 'VBC_U_')
        
        if true_size == 1:
            filtrar_puertos(transistor, component, 'A_drain_T_Hor_', 'VD_T_Hor_')
            filtrar_puertos(transistor, component, 'A_source_T_Hor_', 'VS_T_Hor_')
            filtrar_puertos(transistor, component, 'A_drain_T_Ver_R_', 'VD_T_Ver_R_')
            filtrar_puertos(transistor, component, 'A_drain_T_Ver_L_', 'VD_T_Ver_L_')
            filtrar_puertos(transistor, component, 'A_source_T_Ver_R_', 'VS_T_Ver_R_')
            filtrar_puertos(transistor, component, 'A_source_T_Ver_L_', 'VS_T_Ver_L_')

    if with_b_effect == 1:
        if with_pin == 1:

        ## External o Internal device
 
            #Pin creation
            pin_label_creation('A_drain', 'VD', 'met3', transistor)
            pin_label_creation('A_gate', 'VG', 'met3', transistor)
            pin_label_creation('A_source', 'VS', 'met3', transistor)
            pin_label_creation('bulk_down', 'VB', 'met3', transistor)

        

        component = Component()
        component << transistor

        filtrar_puertos(transistor, component, 'A_drain_', 'VD_')
        filtrar_puertos(transistor, component, 'A_gate_', 'VG_')
        filtrar_puertos(transistor, component, 'A_source_', 'VS_')
        filtrar_puertos(transistor, component, 'bulk_down_', 'VBC_D_')
        filtrar_puertos(transistor, component, 'bulk_up_', 'VBC_U_')
        if true_size == 1:
            filtrar_puertos(transistor, component, 'A_drain_T_Hor_', 'VD_T_Hor_')
            filtrar_puertos(transistor, component, 'A_source_T_Hor_', 'VS_T_Hor_')
            filtrar_puertos(transistor, component, 'A_drain_T_Ver_R_', 'VD_T_Ver_R_')
            filtrar_puertos(transistor, component, 'A_drain_T_Ver_L_', 'VD_T_Ver_L_')
            filtrar_puertos(transistor, component, 'A_source_T_Ver_R_', 'VS_T_Ver_R_')
            filtrar_puertos(transistor, component, 'A_source_T_Ver_L_', 'VS_T_Ver_L_')

    return component

### Single transistor diode primitive ###

def diode(pdk, devices_info, matrix, with_pin: int = 0) -> Component:
    diode = Component()
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    matrix = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose

    Diode primitive, can be used in its NMOS version or PMOS
    """
    #Matrix placement

    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'])
    matrix = diode << config
    diode.add_ports(matrix.get_ports_list())

    # Evaluate the dimensions
    ################################
    size_component = evaluate_bbox(matrix)

    # Routing 
    #####################

    # Gate to Drain (A -> A)
    route_gate_drain_A = diode << L_route(pdk, matrix.ports['A_gate_S'], matrix.ports['A_drain_W'])

    # Bulk routing (Neglecting Body Effect)
    route_bulk_1 = diode << straight_route(pdk, matrix.ports['A_source_N'], matrix.ports['bulk_down_S'], glayer1='met3', glayer2='met3')

    if with_pin == 1:
        #Pin creation
        pin_label_creation('A_drain', 'VD', 'met3', diode)
        pin_label_creation('A_source', 'VS', 'met3', diode)
    

    component = Component()
    component << diode

    filtrar_puertos(diode, component, 'A_drain_', 'VD_')
    filtrar_puertos(diode, component, 'A_source_', 'VS_')

    return component

### Current source primitive ###

def current_source(pdk,devices_info,matrix, with_pin: int = 0, with_b_effect: int = 0, true_size:int = 0) -> Component:
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    matrix = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose
    with_b_effect = Allows to have or not to have a bulk port
    true_size = saves extra ports to rail function, these ports include all the metal to add vias

    Current source primitive, can be used in its NMOS version or PMOS
    """
    current_source = Component()

    #Matrix placement
    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'], full_output_size = true_size)
    matrix = current_source << config
    current_source.add_ports(matrix.get_ports_list())

    # Evaluate the dimensions
    ################################
    size_component = evaluate_bbox(matrix)

    # Routing 
    #####################

    #Gate routing (Gate (A) -> Gate (B))
    extension_gate = pdk.snap_to_2xgrid(size_component[1]/2 + 2*pdk.get_grule('met3')['min_separation']+0.04)
    route_Gate = current_source << c_route(pdk, matrix.ports['A_gate_N'], matrix.ports['B_gate_N'], cglayer='met2', extension = extension_gate)

    if with_b_effect == 0:

        # Bulk routing (Neglecting Body Effect)
        via_ref = via_stack(pdk, 'met2', 'met3')

        via_A_bulk = current_source << via_ref
        via_A_bulk.movex(matrix.ports['A_source_N'].center[0]).movey(matrix.ports['bulk_down_E'].center[1])

        via_B_bulk = current_source << via_ref
        via_B_bulk.movex(matrix.ports['B_source_N'].center[0]).movey(matrix.ports['bulk_down_E'].center[1])

        Route_bulk_1 = current_source << straight_route(pdk, matrix.ports['A_source_N'], via_A_bulk.ports['top_met_N'])
        Route_bulk_2 = current_source << straight_route(pdk, matrix.ports['B_source_N'], via_B_bulk.ports['top_met_N'])

        ## External o Internal device

        if with_pin == 1:
            #Pin creation
            pin_label_creation('A_gate', 'VBIAS', 'met3', current_source)
            pin_label_creation('B_gate', 'VBIAS2', 'met3', current_source)
            pin_label_creation('A_source', 'VS1', 'met3', current_source)
            pin_label_creation('B_source', 'VS2', 'met3', current_source)
            pin_label_creation('A_drain', 'VD1', 'met3', current_source)
            pin_label_creation('B_drain', 'VD2', 'met3', current_source)
            pin_label_creation('bulk_up', 'VBC_U', 'met3',current_source)
            pin_label_creation('bulk_down', 'VBC_D', 'met3',current_source)


        component = Component()
        component << current_source

        filtrar_puertos(current_source, component, 'A_gate_', 'VBIAS_')
        filtrar_puertos(current_source, component, 'B_gate_', 'VBIAS2_')
        filtrar_puertos(current_source, component, 'A_source_', 'VS1_')
        filtrar_puertos(current_source, component, 'B_source_', 'VS2_')
        filtrar_puertos(current_source, component, 'A_drain_', 'VD1_')
        filtrar_puertos(current_source, component, 'B_drain_', 'VD2_')
        filtrar_puertos(current_source, component, 'bulk_up_', 'bulk_up_')
        filtrar_puertos(current_source, component, 'bulk_down_', 'bulk_down_')
        if true_size == 1:
            #horizontals
            filtrar_puertos(current_source, component, 'A_source_T_Hor_', 'VS1_T_Hor_')
            filtrar_puertos(current_source, component, 'B_source_T_Hor_', 'VS2_T_Hor_')
            filtrar_puertos(current_source, component, 'A_drain_T_Hor_', 'VD1_T_Hor_')
            filtrar_puertos(current_source, component, 'B_drain_T_Hor_', 'VD2_T_Hor_')
            #verticals
            filtrar_puertos(current_source, component, 'A_source_T_Ver_R_', 'VS1_T_Ver_R_')
            filtrar_puertos(current_source, component, 'A_source_T_Ver_L_', 'VS1_T_Ver_L_')
            filtrar_puertos(current_source, component, 'B_source_T_Ver_R_', 'VS2_T_Ver_R_')
            filtrar_puertos(current_source, component, 'B_source_T_Ver_L_', 'VS2_T_Ver_L_')
            filtrar_puertos(current_source, component, 'A_drain_T_Ver_R_', 'VD1_T_Ver_R_')
            filtrar_puertos(current_source, component, 'A_drain_T_Ver_L_', 'VD1_T_Ver_L_')
            filtrar_puertos(current_source, component, 'B_drain_T_Ver_R_', 'VD2_T_Ver_R_')
            filtrar_puertos(current_source, component, 'B_drain_T_Ver_L_', 'VD2_T_Ver_L_')
    if with_b_effect == 1:

        ## External o Internal device

        if with_pin == 1:
            #Pin creation
            pin_label_creation('A_gate', 'VBIAS', 'met3', current_source)
            pin_label_creation('B_gate', 'VBIAS2', 'met3', current_source)
            pin_label_creation('A_source', 'VS1', 'met3', current_source)
            pin_label_creation('B_source', 'VS2', 'met3', current_source)
            pin_label_creation('A_drain', 'VD1', 'met3', current_source)
            pin_label_creation('B_drain', 'VD2', 'met3', current_source)
            pin_label_creation('bulk_down', 'V_bulk', 'met3', current_source)

        
        component = Component()
        component << current_source

        filtrar_puertos(current_source, component, 'A_gate_', 'VBIAS_')
        filtrar_puertos(current_source, component, 'B_gate_', 'VBIAS2_')
        filtrar_puertos(current_source, component, 'A_source_', 'VS1_')
        filtrar_puertos(current_source, component, 'B_source_', 'VS2_')
        filtrar_puertos(current_source, component, 'A_drain_', 'VD1_')
        filtrar_puertos(current_source, component, 'B_drain_', 'VD2_')
        filtrar_puertos(current_source, component, 'bulk_down_', 'bulk_down_')
        filtrar_puertos(current_source, component, 'bulk_up_', 'bulk_up_')
        if true_size == 1:
            #horizontals
            filtrar_puertos(current_source, component, 'A_source_T_Hor_', 'VS1_T_Hor_')
            filtrar_puertos(current_source, component, 'B_source_T_Hor_', 'VS2_T_Hor_')
            filtrar_puertos(current_source, component, 'A_drain_T_Hor_', 'VD1_T_Hor_')
            filtrar_puertos(current_source, component, 'B_drain_T_Hor_', 'VD2_T_Hor_')
            #verticals
            filtrar_puertos(current_source, component, 'A_source_T_Ver_R_', 'VS1_T_Ver_R_')
            filtrar_puertos(current_source, component, 'A_source_T_Ver_L_', 'VS1_T_Ver_L_')
            filtrar_puertos(current_source, component, 'B_source_T_Ver_R_', 'VS2_T_Ver_R_')
            filtrar_puertos(current_source, component, 'B_source_T_Ver_L_', 'VS2_T_Ver_L_')
            filtrar_puertos(current_source, component, 'A_drain_T_Ver_R_', 'VD1_T_Ver_R_')
            filtrar_puertos(current_source, component, 'A_drain_T_Ver_L_', 'VD1_T_Ver_L_')
            filtrar_puertos(current_source, component, 'B_drain_T_Ver_R_', 'VD2_T_Ver_R_')
            filtrar_puertos(current_source, component, 'B_drain_T_Ver_L_', 'VD2_T_Ver_L_')
    
    component = center_component_with_ports(pdk, component)
    return component

### Differential pair ###

def differential_pair(pdk,devices_info,matrix, with_pin: int = 0, with_b_effect: int = 0) -> Component:
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    matrix = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose
    with_b_effect = Allows to have or not to have a bulk port

    Differential pair primitive, can be used in its NMOS version or PMOS
    """
    differential_pair = Component()

    #Matrix placement
    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'])
    matrix = differential_pair << config
    differential_pair.add_ports(matrix.get_ports_list())

    # Evaluate the dimensions
    ################################
    size_component = evaluate_bbox(matrix)

    # Routing 
    #####################

    #Routing from Source(A -> B)
    route_source_A_source_B = differential_pair << L_route(pdk, matrix.ports['A_source_N'], matrix.ports['B_source_E'])

    if with_b_effect == 0:
        # Bulk routing (Neglecting Body Effect)
        via_ref = via_stack(pdk, 'met2', 'met3')

        via_A_bulk = differential_pair << via_ref
        via_A_bulk.movex(matrix.ports['A_source_N'].center[0]).movey(matrix.ports['bulk_down_E'].center[1])

        via_B_bulk = differential_pair << via_ref
        via_B_bulk.movex(matrix.ports['B_source_N'].center[0]).movey(matrix.ports['bulk_down_E'].center[1])

        ruta_bulk_1 = differential_pair << straight_route(pdk, matrix.ports['A_source_S'], via_A_bulk.ports['top_met_N'])
        ruta_bulk_2 = differential_pair << straight_route(pdk, matrix.ports['B_source_S'], via_B_bulk.ports['top_met_N'])

        ## External o Internal device

        if with_pin == 1:
            #Pin creation
            pin_label_creation('A_gate', 'VGP', 'met3', differential_pair)
            pin_label_creation('B_gate', 'VGN', 'met3', differential_pair)
            pin_label_creation('A_source', 'VS', 'met3', differential_pair)
            pin_label_creation('A_drain', 'VD1', 'met3', differential_pair)
            pin_label_creation('B_drain', 'VD2', 'met3', differential_pair)

        

        component = Component()
        component << differential_pair
        filtrar_puertos(differential_pair, component, 'A_gate_', 'VGP_')
        filtrar_puertos(differential_pair, component, 'B_gate_', 'VGN_')
        filtrar_puertos(differential_pair, component, 'B_source_', 'VS_')
        filtrar_puertos(differential_pair, component, 'A_drain_', 'VD1_')
        filtrar_puertos(differential_pair, component, 'B_drain_', 'VD2_')
        filtrar_puertos(differential_pair, component, 'bulk_down_', 'VBC_D_')
        filtrar_puertos(differential_pair, component, 'bulk_up_', 'VBC_U_')
    
    if with_b_effect == 1:

        ## External o Internal device

        if with_pin == 1:
            #Pin creation
            pin_label_creation('A_gate', 'VGP', 'met3', differential_pair)
            pin_label_creation('B_gate', 'VGN', 'met3', differential_pair)
            pin_label_creation('A_source', 'VS', 'met3', differential_pair)
            pin_label_creation('A_drain', 'VD1', 'met3', differential_pair)
            pin_label_creation('B_drain', 'VD2', 'met3', differential_pair)
            pin_label_creation('bulk_down', 'VB', 'met3', differential_pair)

        

        component = Component()
        component << differential_pair
        filtrar_puertos(differential_pair, component, 'A_gate_', 'VGP_')
        filtrar_puertos(differential_pair, component, 'B_gate_', 'VGN_')
        filtrar_puertos(differential_pair, component, 'B_source_', 'VS_')
        filtrar_puertos(differential_pair, component, 'A_drain_', 'VD1_')
        filtrar_puertos(differential_pair, component, 'B_drain_', 'VD2_')
        filtrar_puertos(differential_pair, component, 'bulk_down_', 'VBC_D_')
        filtrar_puertos(differential_pair, component, 'bulk_up_', 'VBC_U_')


    return component

#### 2ND LEVEL PRIMITIVES ####

### Cascode ###

def Cascode(pdk, devices_info, array, with_pin: int = 0, true_size: int = 0) -> Component:
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    array = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose
    true_size = saves extra ports to rail function, these ports include all the metal to add vias

    Cascode primitive, can be used in its NMOS version or PMOS
    """
    Cascode = Component()

    # Use of 1st order primitive

    CS1 = current_source(pdk, devices_info[0], array[0], 0, 1, true_size)
    CS2 = current_source(pdk, devices_info[1], array[1], 0, 0, true_size) 

    Current_Source_1 = Cascode << CS1
    Current_Source_2 = Cascode << CS2


    # Placement and size of the current source
    ####################

    size_CS_2 = evaluate_bbox(Current_Source_2)
    size_CS_1 = evaluate_bbox(Current_Source_1)
    max_size = pdk.snap_to_2xgrid(pdk.get_grule('met4')['min_separation'] + (size_CS_1[1]+size_CS_2[1])/2)
    Current_Source_1.movey(pdk.get_grule('met4')['min_separation']+max_size)
    
    Current_Source_1.mirror(p1=(0, 0), p2=(1, 0))
    Current_Source_2.mirror(p1=(0, 0), p2=(1, 0))

    # Centering

    ### Porting ###

    Cascode.add_ports(Current_Source_1.get_ports_list(),prefix='CS1_')
    Cascode.add_ports(Current_Source_2.get_ports_list(),prefix='CS2_')

    # Routing 
    ###################

    ### Diode routing ###
    diode_route = Cascode << c_route(pdk, Current_Source_1.ports['VD1_E'], Current_Source_2.ports['VBIAS2_E'])
    
    ### Between transistors routing ###
    Route_DS1 = Cascode << straight_route(pdk, Current_Source_1.ports['VS1_N'], Current_Source_2.ports['VD1_S'])
    Route_DS2 = Cascode << straight_route(pdk, Current_Source_1.ports['VS2_N'], Current_Source_2.ports['VD2_S'])

    ### Bulk connection ###
    if size_CS_2[0]<=size_CS_1[0]:
        pos_der = (Cascode.ports['CS2_bulk_down_N'].center[0]-Cascode.ports['CS2_bulk_down_W'].center[0])/2
        pos_iz = (Cascode.ports['CS2_bulk_down_N'].center[0]-Cascode.ports['CS2_bulk_down_E'].center[0])/2
    else:
        pos_der = (Cascode.ports['CS1_bulk_down_N'].center[0]-Cascode.ports['CS1_bulk_down_W'].center[0])/2
        pos_iz = (Cascode.ports['CS1_bulk_down_N'].center[0]-Cascode.ports['CS1_bulk_down_E'].center[0])/2

    via_ref = via_stack(pdk, 'met2', 'met3')
    bulk_cs2_iz = Cascode << via_ref
    bulk_cs2_iz.movex(pos_iz).movey(Cascode.ports['CS2_bulk_up_E'].center[1])

    bulk_cs1_iz = Cascode << via_ref
    bulk_cs1_iz.movex(pos_iz).movey(Cascode.ports['CS1_bulk_down_E'].center[1])

    bulk_cs2_der = Cascode << via_ref
    bulk_cs2_der.movex(pos_der).movey(Cascode.ports['CS2_bulk_up_E'].center[1])

    bulk_cs1_der = Cascode << via_ref
    bulk_cs1_der.movex(pos_der).movey(Cascode.ports['CS1_bulk_down_E'].center[1])

    Cascode << straight_route(pdk, bulk_cs2_iz.ports['top_met_N'], bulk_cs1_iz.ports['top_met_S'])
    Cascode << straight_route(pdk, bulk_cs2_der.ports['top_met_N'], bulk_cs1_der.ports['top_met_S'])
    ## External o Internal device

    if with_pin == 1:

        pin_label_creation('CS2_VS1', 'VREF', 'met3', Cascode)
        pin_label_creation('CS2_VD1', 'VIP', 'met3', Cascode)
        pin_label_creation('CS2_VD2', 'VIN', 'met3', Cascode)
        pin_label_creation('CS1_VBIAS', 'VB1', 'met3', Cascode)
        pin_label_creation('CS1_VD1', 'VD1', 'met3', Cascode)
        pin_label_creation('CS1_VD2', 'VOUT', 'met3', Cascode)

    component = Component()
    component << Cascode

    filtrar_puertos(Cascode, component, 'CS2_VS2_', 'VREF_') #Source voltage from current mirror P 
    filtrar_puertos(Cascode, component, 'CS2_VD1_', 'VIP_') #Drain voltage from current mirror P (Left Transistor)
    filtrar_puertos(Cascode, component, 'CS2_VD2_', 'VIN_') #Drain voltage from current mirror P (Right Transistor)
    filtrar_puertos(Cascode, component, 'CS1_VBIAS2_', 'VB1_') #Gate voltage from active load P
    filtrar_puertos(Cascode, component, 'CS2_VBIAS2_', 'VB2_') #Gate voltage from current mirror P 
    filtrar_puertos(Cascode, component, 'CS1_VD1_', 'VD1_') #Drain voltage from active load P (Left Transistor)
    filtrar_puertos(Cascode, component, 'CS1_VD2_', 'VOUT_') #Drain voltage from active load P (Right Transistor)
    if true_size == 1:
        filtrar_puertos(Cascode, component, 'CS2_VS1_T_Hor_', 'VS1_T_Hor_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(Cascode, component, 'CS2_VS2_T_Hor_', 'VS2_T_Hor_')     #Source voltage from current mirror (Right Transistor)
        #Vertical
        filtrar_puertos(Cascode, component, 'CS2_VS1_T_Ver_R_', 'VS1_T_Ver_R_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(Cascode, component, 'CS2_VS1_T_Ver_L_', 'VS1_T_Ver_L_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(Cascode, component, 'CS2_VS2_T_Ver_R_', 'VS2_T_Ver_R_')     #Source voltage from current mirror (Right Transistor)
        filtrar_puertos(Cascode, component, 'CS2_VS2_T_Ver_L_', 'VS2_T_Ver_L_')     #Source voltage from current mirror (Right Transistor)
    component_centered = center_component_with_ports(pdk, component)

    return component_centered

### Bi current source ###

def Bi_current_source(pdk, devices_info, array, with_pin: int = 0, true_size: int = 0) -> Component:
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    array = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose
    true_size = saves extra ports to rail function, these ports include all the metal to add vias

    Bi_current_source primitive, can be used in its NMOS version or PMOS
    """
    Bi_current_source = Component()

    # Use of 1st order primitive

    CS1 = current_source(pdk, devices_info[0], array[0], 0, 0, true_size)
    CS2 = current_source(pdk, devices_info[1], array[1], 0, 1, true_size)

    Current_Source_1 = Bi_current_source << CS1
    Current_Source_2 = Bi_current_source << CS2


    # Placement and size of the current source
    ####################

    size_CS_2 = evaluate_bbox(Current_Source_2)
    size_CS_1 = evaluate_bbox(Current_Source_1)
    max_size = (size_CS_1[1]+size_CS_2[1])/2

    Current_Source_2.movey(pdk.get_grule('met4')['min_separation']+max_size)

    ### Porting ###

    Bi_current_source.add_ports(Current_Source_1.get_ports_list(),prefix='CS1_')
    Bi_current_source.add_ports(Current_Source_2.get_ports_list(),prefix='CS2_')

    # Routing 
    ###################

    ### Between transistors routing ###
    Route_DS1 = Bi_current_source << straight_route(pdk, Current_Source_1.ports['VD1_N'], Current_Source_2.ports['VS1_S'])
    Route_DS2 = Bi_current_source << straight_route(pdk, Current_Source_1.ports['VD2_N'], Current_Source_2.ports['VS2_S'])

    ### Source connections ###

    Route_Ref = Bi_current_source << L_route(pdk, Current_Source_1.ports['VS1_N'], Current_Source_1.ports['VS2_E'])

    ### Bulk connection ###
    if size_CS_2[0]<=size_CS_1[0]:
        pos_der = (Bi_current_source.ports['CS2_bulk_down_N'].center[0]-Bi_current_source.ports['CS2_bulk_down_W'].center[0])/2
        pos_iz = (Bi_current_source.ports['CS2_bulk_down_N'].center[0]-Bi_current_source.ports['CS2_bulk_down_E'].center[0])/2
    else:
        pos_der = (Bi_current_source.ports['CS1_bulk_down_N'].center[0]-Bi_current_source.ports['CS1_bulk_down_W'].center[0])/2
        pos_iz = (Bi_current_source.ports['CS1_bulk_down_N'].center[0]-Bi_current_source.ports['CS1_bulk_down_E'].center[0])/2

    via_ref = via_stack(pdk, 'met2', 'met3')
    bulk_cs2_iz = Bi_current_source << via_ref
    bulk_cs2_iz.movex(pos_iz).movey(Bi_current_source.ports['CS2_bulk_down_E'].center[1])

    bulk_cs1_iz = Bi_current_source << via_ref
    bulk_cs1_iz.movex(pos_iz).movey(Bi_current_source.ports['CS1_bulk_up_E'].center[1])

    bulk_cs2_der = Bi_current_source << via_ref
    bulk_cs2_der.movex(pos_der).movey(Bi_current_source.ports['CS2_bulk_down_E'].center[1])

    bulk_cs1_der = Bi_current_source << via_ref
    bulk_cs1_der.movex(pos_der).movey(Bi_current_source.ports['CS1_bulk_up_E'].center[1])

    Bi_current_source << straight_route(pdk, bulk_cs2_iz.ports['top_met_N'], bulk_cs1_iz.ports['top_met_S'])
    Bi_current_source << straight_route(pdk, bulk_cs2_der.ports['top_met_N'], bulk_cs1_der.ports['top_met_S'])
   
    ## External o Internal device

    if with_pin == 1:

        pin_label_creation('CS1_VD2', 'VOUT', 'met3', Bi_current_source)
        pin_label_creation('CS1_VD1', 'VD1', 'met3', Bi_current_source)
        pin_label_creation('CS2_VD2', 'VCOMM', 'met3', Bi_current_source)
        pin_label_creation('CS1_VBIAS', 'VB2', 'met3', Bi_current_source)
        pin_label_creation('CS2_VBIAS2', 'VB3', 'met3', Bi_current_source)
        pin_label_creation('CS2_VS2', 'VREF', 'met3', Bi_current_source)

    component = Component()
    component << Bi_current_source

    filtrar_puertos(Bi_current_source, component, 'CS2_VD2_', 'VOUT_')
    filtrar_puertos(Bi_current_source, component, 'CS2_VD1_', 'VD1_')
    filtrar_puertos(Bi_current_source, component, 'CS1_VBIAS_', 'VB2_')
    filtrar_puertos(Bi_current_source, component, 'CS1_VBIAS2_', 'VB2R_')
    filtrar_puertos(Bi_current_source, component, 'CS2_VBIAS2_', 'VB3_')
    filtrar_puertos(Bi_current_source, component, 'CS1_VS2_', 'VREF_')
    filtrar_puertos(Bi_current_source, component, 'CS1_VD2_', 'VCOMM_')
    filtrar_puertos(Bi_current_source, component, 'CS1_VD1_', 'VCS1_D1_')
    filtrar_puertos(Bi_current_source, component, 'CS1_bulk_up_', 'bulk_up_')
    filtrar_puertos(Bi_current_source, component, 'CS1_bulk_down_', 'bulk_down_')
    filtrar_puertos(Bi_current_source, component, 'CS2_bulk_up_', 'bulk2_up_')
    filtrar_puertos(Bi_current_source, component, 'CS2_bulk_down_', 'bulk2_down_')
    if true_size == 1:
        #horizontal
        filtrar_puertos(Bi_current_source, component, 'CS1_VS1_T_Hor_', 'VS1_T_Hor_')
        filtrar_puertos(Bi_current_source, component, 'CS1_VS2_T_Hor_', 'VS2_T_Hor_')
        #vertical
        filtrar_puertos(Bi_current_source, component, 'CS1_VS1_T_Ver_R_', 'VS1_T_Ver_R_')
        filtrar_puertos(Bi_current_source, component, 'CS1_VS1_T_Ver_L_', 'VS1_T_Ver_L_')
        filtrar_puertos(Bi_current_source, component, 'CS1_VS2_T_Ver_R_', 'VS2_T_Ver_R_')
        filtrar_puertos(Bi_current_source, component, 'CS1_VS2_T_Ver_L_', 'VS2_T_Ver_L_')

    component_centered = center_component_with_ports(pdk, component)

    return component_centered, size_CS_1, size_CS_2

### Pair bias ###

def Pair_bias(pdk, devices_info, array, with_pin: int = 0, true_size: int = 0) -> Component:
    """"
    pdk = pdk to use
    devices_info = The devices to place, usually formed as an array with all the information
    array = A full matrix with the placement organization
    with_pin = Makes the primitive have pins which don't have any electrical purpose

    Pair_bias primitive, can be used in its NMOS version or PMOS
    """
    Pair_bias = Component()

    # Use of 1st order primitive
    device_info_par = devices_info[0]
    device_info_tail = devices_info[1]

    P1 = differential_pair(pdk, device_info_par, array[0], 0, 1)
    T1 = transistor(pdk, device_info_tail, array[1], 0, 0, true_size)

    Pair = Pair_bias << P1
    Tail = Pair_bias << T1
    
    # Placement and size of pair and tail
    ####################

    size_P1 = evaluate_bbox(Pair)
    size_T1 = evaluate_bbox(Tail)
    max_size = (size_P1[1] + size_T1[1])/2
    
    Pair.movey(pdk.get_grule('met4')['min_separation']+max_size)
    ### Porting ###
    Pair_bias.add_ports(Pair.get_ports_list(),prefix='P1_')
    Pair_bias.add_ports(Tail.get_ports_list(),prefix='T1_')
    # Routing 
    ###################
    Route_SD = Pair_bias << L_route(pdk, Pair.ports['VS_S'], Tail.ports['VD_E'])    

    if with_pin == 1:

        pin_label_creation('P1_VGP', 'VGP', 'met3', Pair_bias)
        pin_label_creation('P1_VGN', 'VGN', 'met3', Pair_bias)
        pin_label_creation('P1_VD1', 'VDP', 'met3', Pair_bias)
        pin_label_creation('P1_VD2', 'VDN', 'met3', Pair_bias)
        pin_label_creation('T1_VG', 'VBIAS', 'met3', Pair_bias)
        pin_label_creation('T1_VS', 'VREF', 'met3', Pair_bias)

    

    component = Component()
    component << Pair_bias

    filtrar_puertos(Pair_bias, component, 'P1_VGP_', 'VGP_')
    filtrar_puertos(Pair_bias, component, 'P1_VGN_', 'VGN_')
    filtrar_puertos(Pair_bias, component, 'P1_VD1_', 'VDP_')
    filtrar_puertos(Pair_bias, component, 'P1_VD2_', 'VDN_')
    filtrar_puertos(Pair_bias, component, 'P1_VBC_D_', 'P_VBC_D_')
    filtrar_puertos(Pair_bias, component, 'P1_VBC_U_', 'P_VBC_U_')
    filtrar_puertos(Pair_bias, component, 'T1_VG_', 'VBIAS_')
    filtrar_puertos(Pair_bias, component, 'T1_VS_', 'VREF_')
    filtrar_puertos(Pair_bias, component, 'T1_VBC_D_', 'T_VBC_D_')
    filtrar_puertos(Pair_bias, component, 'T1_VBC_U_', 'T_VBC_U_')
    if true_size == 1:
        filtrar_puertos(Pair_bias, component, 'T1_VS_T_Ver_R_', 'T_VS_T_Ver_R_')
        filtrar_puertos(Pair_bias, component, 'T1_VS_T_Ver_L_', 'T_VS_T_Ver_L_')

    component_centered = center_component_with_ports(pdk, component)
    return component_centered, size_P1, size_T1

### MOSCAP ###

def moscap(pdk,devices_info, matrix):
    moscap = Component()
    """"
    description
    """

    #Matrix placement
    config = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info['type'], with_substrate_tap=devices_info['with_substrate_tap'],
                                                              with_tie=devices_info['with_tie'], width1=devices_info['width'], length1=devices_info['length'],
                                                              fingers1=devices_info['fingers'], matriz=matrix, with_dummy=devices_info['with_dummy'],
                                                              width_route_mult=devices_info['width_route_mult'], with_lvt_layer=devices_info['lvt'])

    matrix = moscap << config
    moscap.add_ports(matrix.get_ports_list())

    # Routing 
    #####################

    # Bulk to source connection

    # route_bulk_1 = moscap << L_route(pdk, matrix.ports['A_source_N'], matrix.ports['bulk_down_E'])
    route_drain_source = moscap << straight_route(pdk, matrix.ports['A_drain_N'], matrix.ports['A_source_S'])
    ruta_bulk_cap = moscap << straight_route(pdk, matrix.ports['bulk_up_S'], matrix.ports['A_drain_N'], width=0.5)
    component = Component()
    component << moscap

    filtrar_puertos(moscap, component, 'A_drain_', 'VD_')
    filtrar_puertos(moscap, component, 'A_source_', 'VS_')
    filtrar_puertos(moscap, component, 'A_gate_', 'VG_')

    return component

    ## External o Internal device

# Folded Cascode OTA
---
This code automates the layout generation of the core of a CMOS operational transconductance amplifier (OTA) using previously defined second-level primitives. The functions place_cascode, place_bi_current, and place_par_bias instantiate and parameterize, respectively, the active-load cascode block, the current source, and the differential pair, adapting interdigitated matrices, device widths and lengths, and technological configurations for each element.

The OTA_Core function integrates these three blocks into a single physical structure, computes their relative placement to comply with the PDK’s design rules, performs the internal routing between functional nodes (differential inputs, bias nodes, outputs, VDD, and VSS), and creates standardized input/output ports as well as connection points to power rails. Finally, the generator_core function generates the complete OTA core component along with the list of routes associated with the power rails, leaving it ready for export or integration into higher levels of the design hierarchy.

In [9]:
def place_cascode(pdk: MappedPDK, true_size: int = 0) -> Component:
    place_cascode = Component()

    # Use of second order primitive
    # We define the parameters of our primitive

    m1 = {'type':'pfet', 'name':'M3_M4', 'width':2.00, 'length':1.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':True}
    m2 = {'type':'pfet', 'name':'M5_M6', 'width':2.00, 'length':1.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':True}

    array = [[[2,1],[1,2]], [[1,2]]]
    
    casc_dum_down = (len(array[0][0])+2) * 2 + 2*len(array[0])
    casc_dum_up = (len(array[1][0])+2) * 2 + 2*len(array[1])

    print(f'Casc dum up = {casc_dum_up}')
    print(f'Casc dum down = {casc_dum_down}')

    devices_info = [m1,m2]

    # We call the cascode primitive 
    Cascode_call = Cascode(pdk,devices_info,array, 0, true_size) #No pin, yes true size

    
    Cascode_component = place_cascode << Cascode_call

    place_cascode.add_ports(Cascode_component.get_ports_list(),prefix='CASC_')

    place_cascode_centered = center_component_with_ports(pdk, place_cascode)
    component = Component()
    component << place_cascode_centered

    filtrar_puertos(place_cascode_centered, component, 'CASC_VREF_', 'VREF_') #Source voltage from current mirror P 
    filtrar_puertos(place_cascode_centered, component, 'CASC_VIP_', 'VIP_') #Drain voltage from current mirror P (Left Transistor)
    filtrar_puertos(place_cascode_centered, component, 'CASC_VIN_', 'VIN_') #Drain voltage from current mirror P (Right Transistor)
    filtrar_puertos(place_cascode_centered, component, 'CASC_VB1_', 'VB1_') #Gate voltage from active load P
    filtrar_puertos(place_cascode_centered, component, 'CASC_VB2_', 'VB2_') #Gate voltage from current mirror P 
    filtrar_puertos(place_cascode_centered, component, 'CASC_VD1_', 'VD1_') #Drain voltage from active load P (Left Transistor)
    filtrar_puertos(place_cascode_centered, component, 'CASC_VOUT_', 'VOUT_') #Drain voltage from active load P (Right Transistor)
    if true_size == 1:
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS1_T_Hor_', 'VS1_T_Hor_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS2_T_Hor_', 'VS2_T_Hor_')     #Source voltage from current mirror (Right Transistor)
        #vertical
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS1_T_Ver_R_', 'VS1_T_Ver_R_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS1_T_Ver_L_', 'VS1_T_Ver_L_')     #Source voltage from current mirror (Left Transistor)
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS2_T_Ver_R_', 'VS2_T_Ver_R_')     #Source voltage from current mirror (Right Transistor)
        filtrar_puertos(place_cascode_centered, component, 'CASC_VS2_T_Ver_L_', 'VS2_T_Ver_L_')     #Source voltage from current mirror (Right Transistor)
    return component

def place_bi_current(pdk: MappedPDK, true_size: int = 0) -> Component:
    place_bi_current = Component()

    # Use of second order primitive
    
    m1 = {'type':'nfet', 'name':'M9_M10', 'width':2.00, 'length':2.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':False}
    m2 = {'type':'nfet', 'name':'M7_M8', 'width':2.00, 'length':2.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':False}
    #m1 son los que van a vss
    array = array = [[[1,2],[2,1]],
                     [[1,2],[2,1]]
                      ]

    bi_cur_dum_down = (len(array[0][0])+2) * 2 + 2*len(array[0])
    bi_cur_dum_up = (len(array[1][0])+2) * 2 + 2*len(array[1])

    print(f'bi_cur_dum_up = {bi_cur_dum_up}')
    print(f'bi_cur_dum_down = {bi_cur_dum_down}')


    devices_info = [m1,m2]

    # We call the Bi_current primitive 
    Bi_current_call, size_cs1, size_cs2 = Bi_current_source(pdk,devices_info,array, 0, 1)

    Bi_current_component = place_bi_current << Bi_current_call

    place_bi_current.add_ports(Bi_current_component.get_ports_list(),prefix='BIC_')

    place_bi_current_centered = center_component_with_ports(pdk, place_bi_current)
    component = Component()
    component << place_bi_current_centered

    filtrar_puertos(place_bi_current_centered, component, 'BIC_VOUT_', 'VOUT_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VD1_', 'VD1_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VB2_', 'VB2_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VB2R_', 'VB2R_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VCS1_D1_', 'CS1_VD1_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VB3_', 'VB3_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VREF_', 'VREF_')
    filtrar_puertos(place_bi_current_centered, component, 'BIC_VCOMM_', 'VCOMM_')
    if true_size == 1:
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS1_T_Hor_', 'VS1_T_Hor_')
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS2_T_Hor_', 'VS2_T_Hor_')
        #vertical
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS1_T_Ver_R_', 'VS1_T_Ver_R_')
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS1_T_Ver_L_', 'VS1_T_Ver_L_')
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS2_T_Ver_R_', 'VS2_T_Ver_R_')
        filtrar_puertos(place_bi_current_centered, component, 'BIC_VS2_T_Ver_L_', 'VS2_T_Ver_L_')
    return component, size_cs1, size_cs2

def place_par_bias(pdk: MappedPDK, true_size: int = 0) -> Component:
    place_par_bias = Component()

    # Use of second order primitive

    m1 = {'type':'nfet', 'name':'M1_M2', 'width':2.00, 'length':4.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':False}
    m2 = {'type':'nfet', 'name':'M11', 'width':2.00, 'length':2.00, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'width_route_mult':1, 'lvt':False}

    #Par bias
    array = [[
   	         [1,2,2,1,1,2,2,1,1,2,2,1,1,2,2,1,1,2,2,1],
             [2,1,1,2,2,1,1,2,2,1,1,2,2,1,1,2,2,1,1,2],
             [1,2,2,1,1,2,2,1,1,2,2,1,1,2,2,1,1,2,2,1]
             ]
            ,[[1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1]
              ]] #

    par = (len(array[0][0])+2) * 2 + 2*len(array[0])
    bias = (len(array[1][0])+2) * 2 + 2*len(array[1])

    print(f'Par = {par}')
    print(f'Bias = {bias}')

    devices_info = [m1,m2]

    # We call the Bi_current primitive 
    Par_bias_call, size_P1, size_T1 = Pair_bias(pdk,devices_info,array, 0, true_size)

    Par_bias_component = place_par_bias << Par_bias_call

    place_par_bias.add_ports(Par_bias_component.get_ports_list(),prefix='PBI_')

    #routing bulks
    if size_P1[0]<=size_T1[0]:
        pos_der = (place_par_bias.ports['PBI_P_VBC_D_N'].center[0]-place_par_bias.ports['PBI_P_VBC_D_W'].center[0])/2
        pos_iz = (place_par_bias.ports['PBI_P_VBC_D_N'].center[0]-place_par_bias.ports['PBI_P_VBC_D_E'].center[0])/2
    else:
        pos_der = (place_par_bias.ports['PBI_T_VBC_D_N'].center[0]-place_par_bias.ports['PBI_T_VBC_D_W'].center[0])/2
        pos_iz = (place_par_bias.ports['PBI_T_VBC_D_N'].center[0]-place_par_bias.ports['PBI_T_VBC_D_E'].center[0])/2
    via_ref = via_array(pdk, 'met2', 'met3', (pos_der/2, 0.5))

    bulk_par_1 = place_par_bias << via_ref
    bulk_par_1.movex(pos_der).movey(place_par_bias.ports['PBI_P_VBC_D_E'].center[1])

    bulk_par_2 = place_par_bias << via_ref
    bulk_par_2.movex(pos_iz).movey(place_par_bias.ports['PBI_P_VBC_D_E'].center[1])

    bulk_tail_1 = place_par_bias << via_ref
    bulk_tail_1.movex(pos_der).movey(place_par_bias.ports['PBI_T_VBC_U_E'].center[1])

    bulk_tail_2 = place_par_bias << via_ref
    bulk_tail_2.movex(pos_iz).movey(place_par_bias.ports['PBI_T_VBC_U_E'].center[1])

    place_par_bias << straight_route(pdk, bulk_par_1.ports['top_met_N'], bulk_tail_1.ports['top_met_S'])
    place_par_bias << straight_route(pdk, bulk_par_2.ports['top_met_N'], bulk_tail_2.ports['top_met_S'])

    place_par_bias_centered = center_component_with_ports(pdk, place_par_bias)
    component = Component()
    component << place_par_bias_centered

    filtrar_puertos(place_par_bias_centered, component, 'PBI_VGP_', 'VGP_')
    filtrar_puertos(place_par_bias_centered, component, 'PBI_VGN_', 'VGN_')
    filtrar_puertos(place_par_bias_centered, component, 'PBI_VDP_', 'VDP_')
    filtrar_puertos(place_par_bias_centered, component, 'PBI_VDN_', 'VDN_')
    filtrar_puertos(place_par_bias_centered, component, 'PBI_VBIAS_', 'VBIAS_')
    filtrar_puertos(place_par_bias_centered, component, 'PBI_VREF_', 'VREF_')
    if true_size:
        filtrar_puertos(place_par_bias_centered, component, 'PBI_T_VS_T_Ver_L_', 'T_VS_T_Ver_L_')
        filtrar_puertos(place_par_bias_centered, component, 'PBI_T_VS_T_Ver_R_', 'T_VS_T_Ver_R_')

    return component, devices_info

def OTA_Core(pdk: MappedPDK) -> Component:
    OTA_core = Component()

    BI1, size_c1, size_c2 = place_bi_current(pdk, 1)
    CAS1= place_cascode(pdk, 1)
    PB1, type_par = place_par_bias(pdk, 1)

    TOP_BI1 = OTA_core << BI1
    TOP_CAS1 = OTA_core << CAS1
    TOP_PB1 = OTA_core << PB1
    
    size_BI1 = evaluate_bbox(TOP_BI1)
    size_CAS1 = evaluate_bbox(TOP_CAS1)
    size_PB1 = evaluate_bbox(TOP_PB1)

    print(size_BI1)
    print(size_CAS1)

    max_size_y = pdk.snap_to_2xgrid((size_BI1[1] + size_CAS1[1])/2)
    if size_CAS1[0]>size_BI1[0]:
        max_size_x = pdk.snap_to_2xgrid((size_CAS1[0] + size_PB1[0])/2)
    else:
        max_size_x = pdk.snap_to_2xgrid((size_BI1[0] + size_PB1[0])/2)
    mov_par_tail = pdk.snap_to_2xgrid(((size_PB1[1] - size_BI1[1])/2)-0.01)

    if type_par[0]['type']=='nfet':
    
        TOP_CAS1.movey(max_size_y +pdk.get_grule('met3')['min_separation'])
        TOP_PB1.movey(mov_par_tail)
        TOP_PB1.movex(-(max_size_x+2*pdk.get_grule('met3')['min_separation']))

        OTA_core.add_ports(TOP_BI1.get_ports_list(),prefix='BI_')
        OTA_core.add_ports(TOP_CAS1.get_ports_list(),prefix='CAS_')
        OTA_core.add_ports(TOP_PB1.get_ports_list(),prefix='PB_')
        
        #Routing
        Route_VDS1 = OTA_core << c_route(pdk, TOP_BI1.ports['VD1_W'], TOP_CAS1.ports['VD1_W'])
        Route_VDS2 = OTA_core << c_route(pdk, TOP_BI1.ports['VOUT_E'], TOP_CAS1.ports['VOUT_E'])

        Route_CN = OTA_core << L_route(pdk, TOP_PB1.ports['VDN_S'], TOP_CAS1.ports['VIN_W'])
        Route_CP = OTA_core << L_route(pdk, TOP_PB1.ports['VDP_S'], TOP_CAS1.ports['VIP_W'])
        lower_position = max(
                            abs(TOP_PB1.ports['VBIAS_S'].center[1]),
                            abs(TOP_BI1.ports['VB2_S'].center[1])
                            )
        size_component = -1*OTA_core.bbox[0][1]
        extension_bias = pdk.get_grule('met2')['min_separation'] + (size_component - lower_position)
        Route_Bias = OTA_core << c_route(pdk, TOP_PB1.ports['VBIAS_S'],TOP_BI1.ports['VB2_S'], cglayer='met2', extension=extension_bias)
        Route_VSS = OTA_core << c_route(pdk, TOP_PB1.ports['VREF_S'], TOP_BI1.ports['VREF_S'], cglayer='met2', extension=0.5 + 2*pdk.get_grule('met2')['min_separation'])

    else:
        TOP_PB1.mirror((1,0))
        TOP_CAS1.movey(max_size_y +pdk.get_grule('met3')['min_separation'])
        TOP_PB1.movey((max_size_y +pdk.get_grule('met3')['min_separation'])-(pdk.snap_to_2xgrid((size_PB1[1] - size_CAS1[1])/2))+0.01)
        TOP_PB1.movex(-(max_size_x+2*pdk.get_grule('met3')['min_separation']))

        OTA_core.add_ports(TOP_BI1.get_ports_list(),prefix='BI_')
        OTA_core.add_ports(TOP_CAS1.get_ports_list(),prefix='CAS_')
        OTA_core.add_ports(TOP_PB1.get_ports_list(),prefix='PB_')

        #Routing
        Route_VDS1 = OTA_core << c_route(pdk, TOP_BI1.ports['VD1_W'], TOP_CAS1.ports['VD1_W'])
        Route_VDS2 = OTA_core << c_route(pdk, TOP_BI1.ports['VOUT_E'], TOP_CAS1.ports['VOUT_E'])

        Route_D1Par_D1M9 = OTA_core << L_route(pdk, TOP_PB1.ports['VDN_N'], TOP_BI1.ports['CS1_VD1__E'])
        Route_D2Par_D2M10 = OTA_core << L_route(pdk, TOP_PB1.ports['VDP_N'], TOP_BI1.ports['VCOMM_E'])
        Route_VDD = OTA_core << c_route(pdk, TOP_PB1.ports['VREF_S'], TOP_CAS1.ports['VREF_S'], extension=3*pdk.get_grule('met3')['min_separation'])
        OTA_core.add_ports(Route_VDD.get_ports_list(), prefix='Ruta_')

    # Centered
    OTA_core_centered = center_component_with_ports(pdk, OTA_core)

    boundary_dim = evaluate_bbox(OTA_core_centered)

    save_ports_component =  Component()

    #Input/Output port 
    min_separation_met3 = pdk.get_grule('met3')['min_separation']
    rectangle_ref = rectangle((0.5,0.5), layer=pdk.get_glayer('met2'), centered=True)
    aux_via_ref = via_stack(pdk, 'met2', 'met3')

    size_output = evaluate_bbox(rectangle_ref)
    size_aux = evaluate_bbox(aux_via_ref)
    if size_c1[0] + min_separation_met3 > size_c2[0]:
        size_aux1 = (size_c1[0]-size_c2[0])/2
    else:
        size_aux1 = 0
    if size_BI1[0] + min_separation_met3 > size_CAS1[0]:
        size_axu2 = (size_BI1[0]-size_CAS1[0])/2
    else:
        size_axu2 = 0
    
    VbiasP2 = OTA_core_centered << rectangle_ref
    pos_movey = -boundary_dim[1]/2 - 3*pdk.get_grule('met2')['min_separation'] - 5*evaluate_bbox(rectangle_ref)[0]/2
    VbiasP2.movey(pdk.snap_to_2xgrid(pos_movey))
    VbiasP2.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    ##aux rect
    via_axu_biasP2 = OTA_core_centered << aux_via_ref
    via_axu_biasP2.movey(OTA_core_centered.ports['CAS_VB1_E'].center[1])
    via_axu_biasP2.movex(evaluate_bbox(OTA_core_centered)[0]/2 + size_aux[0]*3/2 + 2*min_separation_met3)
    OTA_core_centered << straight_route(pdk, OTA_core_centered.ports['CAS_VB1_E'], via_axu_biasP2.ports['bottom_met_E'])
    OTA_core_centered << L_route(pdk, via_axu_biasP2.ports['top_met_N'], VbiasP2.ports['e3'])
    save_ports_component.add_ports(VbiasP2.get_ports_list(), prefix='VbiasP2_')

    VbiasN2 = OTA_core_centered << rectangle_ref
    pos_movey = -boundary_dim[1]/2 - 2*pdk.get_grule('met2')['min_separation'] - 3*evaluate_bbox(rectangle_ref)[0]/2
    VbiasN2.movey(pdk.snap_to_2xgrid(pos_movey))
    VbiasN2.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    OTA_core_centered << c_route(pdk, OTA_core_centered.ports['BI_VB3_E'], VbiasN2.ports['e3'], extension=size_aux1+pdk.get_grule('met3')['min_separation'])
    save_ports_component.add_ports(VbiasN2.get_ports_list(), prefix='VbiasN2_')

    VbiasN1 = OTA_core_centered << rectangle_ref
    VbiasN1.movey(pdk.snap_to_2xgrid(OTA_core_centered.ports['PB_VBIAS_W'].center[1]))
    VbiasN1.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    OTA_core_centered << straight_route(pdk, OTA_core_centered.ports['PB_VBIAS_E'], VbiasN1.ports['e1'])
    save_ports_component.add_ports(VbiasN1.get_ports_list(), prefix='VbiasN1_')

    V_neg = OTA_core_centered << rectangle_ref
    pos_movey = OTA_core_centered.ports['PB_VDN_E'].center[1] + pdk.get_grule('met2')['min_separation'] + size_output[1]
    V_neg.movey(pdk.snap_to_2xgrid(pos_movey))
    V_neg.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    OTA_core_centered << L_route(pdk, OTA_core_centered.ports['PB_VGN_S'], V_neg.ports['e1'])
    save_ports_component.add_ports(V_neg.get_ports_list(), prefix='V_neg_')

    V_comn = OTA_core_centered << rectangle_ref
    V_comn.movey(pdk.snap_to_2xgrid(OTA_core_centered.ports['BI_VCOMM_W'].center[1]))
    V_comn.movex((pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    OTA_core_centered << straight_route(pdk, OTA_core_centered.ports['BI_VCOMM_W'], V_comn.ports['e3'])
    save_ports_component.add_ports(V_comn.get_ports_list(), prefix='V_comn_')

    V_out = OTA_core_centered << rectangle_ref
    V_out.movey(pdk.snap_to_2xgrid(OTA_core_centered.ports['CAS_VOUT_W'].center[1]))
    V_out.movex((pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    OTA_core_centered << straight_route(pdk, OTA_core_centered.ports['CAS_VOUT_W'], V_out.ports['e3'])
    save_ports_component.add_ports(V_out.get_ports_list(), prefix='V_out_')

    rename_ports_by_orientation(save_ports_component)
    OTA_core_centered.add_ports(save_ports_component.ports)
    #Centered and boundary
    OTA_core_centered = center_component_with_ports(pdk, OTA_core_centered)

    #Rails

    route_list=[['PB_T_VS_T_Ver_L_', 'VSS'], ['PB_T_VS_T_Ver_R_', 'VSS'], ['BI_VS1_T_Ver_L_', 'VSS'], ['BI_VS1_T_Ver_R_', 'VSS'],  ['BI_VS2_T_Ver_L_', 'VSS'], ['BI_VS2_T_Ver_R_', 'VSS'],
                 ['CAS_VS1_T_Ver_L_', 'VDD'], ['CAS_VS1_T_Ver_R_', 'VDD'], ['CAS_VS2_T_Ver_L_', 'VDD'], ['CAS_VS2_T_Ver_R_', 'VDD']]
    
    #Save ports
    component = Component()
    component << OTA_core_centered

    filtrar_puertos(OTA_core_centered, component, 'PB_VGP_', 'P_V+_', True)
    filtrar_puertos(OTA_core_centered, component, 'V_neg_', 'P_V-_', True)
    filtrar_puertos(OTA_core_centered, component, 'VbiasN1_', 'P_VbiasN1_', True) 
    filtrar_puertos(OTA_core_centered, component, 'V_out_', 'P_Vout_', True)
    filtrar_puertos(OTA_core_centered, component, 'VbiasP2_', 'P_VbiasP2_', True) 
    filtrar_puertos(OTA_core_centered, component, 'VbiasN2_', 'P_VbiasN2_', True)  
    filtrar_puertos(OTA_core_centered, component, 'V_comn_', 'P_Vcomn_', True)
    for route in route_list:
        filtrar_puertos(OTA_core_centered, component, route[0])

    return component_snap_to_grid(component), route_list

def generator_core():
    Test, route_list = OTA_Core(gf180)
    #Test.name = "error_amplifier_N_input_core"
    #Test.write_gds("error_amplifier_N_input_core_pcells.gds")
    #Test.show()
    #display_component(Test, "error_amplifier_N_input_core_pcells")
    return Test, route_list

#if __name__ == "__main__":
    # If called directly call main function
    # generator_core()

# Current Reference generation

This code implements the automatic layout generation of a complete current reference, including its output branches and compensation elements. The current_reference function places and routes the reference transistors (P and N) based on interdigitated matrices and technological parameters, creates and connects the associated current mirrors to obtain multiple programmable current outputs (IREFp and IREFn), and optionally adds compensating MOSCAPs when the total number of P and N branches does not match, ensuring area balance and electrical compatibility.

Within the block, all internal connections among gates, drains, sources, bodies, and the MOS capacitor are resolved. The function also generates the main external nodes (current reference outputs, operational amplifier output, negative reference, resistor node, and common node) and defines the ports required for power-rail connections (VDD and VSS).

The generator_current_reference function specifies a particular configuration of devices, matrices, and mirror factors, invokes current_reference, and returns the layout component of the current reference along with the list of routes to the power rails, making it ready for integration into higher levels of the design.

In [10]:
def current_reference(pdk, devices_info, matriz_ref, matriz_p, matriz_n, p_mirrors, n_mirrors, MC_array, moscaps) -> Component:
    
    current_reference = Component()
    T1 = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info[0]['type'], with_substrate_tap=devices_info[0]['with_substrate_tap'],
                                                              with_tie=devices_info[0]['with_tie'], width1=devices_info[0]['width'], length1=devices_info[0]['length'],
                                                              fingers1=devices_info[0]['fingers'], matriz=matriz_ref, with_dummy=devices_info[0]['with_dummy'],
                                                              width_route_mult=devices_info[0]['width_route_mult'], with_lvt_layer=devices_info[0]['lvt'], full_output_size = True)

    T2 = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info[1]['type'], with_substrate_tap=devices_info[1]['with_substrate_tap'],
                                                              with_tie=devices_info[1]['with_tie'], width1=devices_info[1]['width'], length1=devices_info[1]['length'],
                                                              fingers1=devices_info[1]['fingers'], matriz=matriz_p, with_dummy=devices_info[1]['with_dummy'],
                                                              width_route_mult=devices_info[1]['width_route_mult'], with_lvt_layer=devices_info[1]['lvt'], full_output_size = True)

    T5 = macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info[2]['type'], with_substrate_tap=devices_info[2]['with_substrate_tap'],
                                                              with_tie=devices_info[2]['with_tie'], width1=devices_info[2]['width'], length1=devices_info[2]['length'],
                                                              fingers1=devices_info[2]['fingers'], matriz=matriz_n, with_dummy=devices_info[2]['with_dummy'],
                                                              width_route_mult=devices_info[2]['width_route_mult'], with_lvt_layer=devices_info[2]['lvt'], full_output_size = True)
    
    MC = moscap(gf180, devices_info[3], MC_array)

    print('Transistores de referencia creados')

    Tref = current_reference << T1
    Pref = current_reference << T2
    Nref = current_reference << T5
    Tmoscap = current_reference << MC
    
    size_Tref = evaluate_bbox(Tref)
    size_Pref = evaluate_bbox(Pref)
    size_Nref = evaluate_bbox(Nref)
    size_Tmoscap = evaluate_bbox(Tmoscap)

    # Width configuration
    width_route = devices_info[0]['width_route_mult']
    if width_route == None or width_route == 0:
        separation_interdigitado = 0
        width_horizontal = evaluate_bbox(via_stack(pdk,'met2','met3'))[1]
    else:
        separation_interdigitado = width_route
        width_horizontal = width_route

    size_via = evaluate_bbox(via_stack(pdk, 'met3', 'met4'))
    

    pmove_x = pdk.snap_to_2xgrid(pdk.get_grule('met4')['min_separation'] + (size_Tref[0] + size_Pref[0])/2)
    nmove_x = pdk.snap_to_2xgrid((size_Nref[0] - size_Tref[0])/2)
    moscapmovex = pdk.snap_to_2xgrid((size_Tmoscap[0]-size_Tref[0])/2)

    #pmove_y = pdk.snap_to_2xgrid(pdk.get_grule('met4')['min_separation']/2 + size_Pref[1]/2)
    if size_Tref[1]>= size_Pref[1]:
        nmove_y = pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + (size_Tref[1] + size_Nref[1])/2)
        moscapmovey = pdk.snap_to_2xgrid(4*pdk.get_grule('met4')['min_separation'] + + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + size_Tref[1]/2 + size_Nref[1] + size_Tmoscap[1]/2)
    else:
        nmove_y = pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + (size_Pref[1] + size_Nref[1])/2)
        moscapmovey = pdk.snap_to_2xgrid(4*pdk.get_grule('met4')['min_separation'] + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + size_Pref[1]/2 + size_Nref[1] + size_Tmoscap[1]/2)

    type_transistor_p = 0
    for transistor in matriz_p[0]:
        if transistor==1:
            type_transistor_p+=1
    
    Pref.movex(pmove_x)
    Nref.mirror((1,0))
    Nref.movex(nmove_x).movey(-nmove_y)
    Tmoscap.movex(moscapmovex).movey(-moscapmovey)

    '''type_transistor_n = 0
    for transistor in matriz_n[0]:
        if transistor==1:
            type_transistor_n+=1'''

    #Conexiones del transistor Tref consigo mismo
    extensionTref = abs(Tref.ports['B_source_S'].center[1]-Tref.ports['A_gate_S'].center[1]) + pdk.get_grule('met2')['min_separation']
    rutagrefAgrefB = current_reference << c_route(pdk, Tref.ports['A_gate_S'], Tref.ports['B_gate_S'] ,extension=extensionTref, cglayer='met2')
    rutadrefAsrefB = current_reference << L_route(pdk, Tref.ports['A_drain_W'], Tref.ports['B_source_S'])
    rutabrefsref = current_reference << straight_route(pdk, Tref.ports['bulk_down_N'], Tref.ports['A_source_S'])

    #Conexiones del transistor Pref consigo mismo
    extensionPref = abs(Pref.ports['B_source_S'].center[1]-Pref.ports['A_gate_S'].center[1]) + pdk.get_grule('met2')['min_separation']
    rutagpAgpB = current_reference << c_route(pdk, Pref.ports['A_gate_S'], Pref.ports['B_gate_S'], extension=extensionPref, cglayer='met2')
    rutadpAspB = current_reference << L_route(pdk, Pref.ports['A_drain_W'], Pref.ports['B_source_S'])
    rutaprefsref = current_reference << straight_route(pdk, Pref.ports['bulk_down_N'], Pref.ports['A_source_S'])

    #Conexiones del transistor Nref consigo mismo
    extensionNref = abs(Nref.ports['B_source_S'].center[1]-Nref.ports['A_gate_S'].center[1]) + pdk.get_grule('met2')['min_separation']
    rutagnAgnB = current_reference << c_route(pdk, Nref.ports['A_gate_S'], Nref.ports['B_gate_S'], extension=extensionNref, cglayer='met2')
    rutasnBdnA = current_reference << L_route(pdk, Nref.ports['B_source_N'], Nref.ports['A_drain_W'])
    rutadnBgnB = current_reference << L_route(pdk, Nref.ports['B_drain_W'], Nref.ports['A_gate_N'])
    rutanrefsref = current_reference << straight_route(pdk, Nref.ports['bulk_down_N'], Nref.ports['A_source_S'])

    #Ports para conexión dp_gn
    #input port
    via_dp = via_stack(pdk, 'met2', 'met3')
    V_dp = current_reference << via_dp
    align_comp_to_port(V_dp, Pref.ports['B_drain_N'])
    size_via = evaluate_bbox(via_stack(pdk, 'met2', 'met3'))
    if size_Tref[1]<=size_Pref[1]:
        min_separation = pdk.get_grule('met3')['min_separation']
    else:
        min_separation = pdk.get_grule('met3')['min_separation'] + (size_Tref[1]-size_Pref[1])/2
    V_dp.movey(pdk.snap_to_2xgrid(min_separation))

    via_gn = via_stack(pdk, 'met2', 'met3')
    V_gn = current_reference << via_gn
    align_comp_to_port(V_gn, Nref.ports['A_gate_W'])
    size_via = evaluate_bbox(via_stack(pdk, 'met2', 'met3'))
    min_separation = pdk.get_grule('met3')['min_separation']
    V_gn.movex(pdk.snap_to_2xgrid(-min_separation))
    
    #Conexiones de los transistores referencia
    if size_Tref==size_Pref:
        ruta_gref_gp = current_reference << straight_route(pdk, Tref.ports['B_gate_W'], Pref.ports['A_gate_E'])
    else:
        ruta_gref_gp = current_reference << c_route(pdk, Tref.ports['B_gate_N'], Pref.ports['A_gate_N'], cglayer='met2')
    ruta_viadp_dp = current_reference << straight_route(pdk, V_dp.ports['bottom_met_N'], Pref.ports['B_drain_S'])
    ruta_viagn_gn = current_reference << straight_route(pdk, V_gn.ports['top_met_W'], Nref.ports['A_gate_E'])
    ruta_dp_gn = current_reference << L_route(pdk, V_dp.ports['bottom_met_E'], V_gn.ports['bottom_met_N'], vglayer='met3')
    ruta_moscap_Tref = current_reference << c_route(pdk, Tref.ports['B_drain_W'], Tmoscap.ports['VG_W'], extension=pdk.snap_to_2xgrid(0.7))

    current_reference.add_ports(V_dp.ports, prefix = 'Vdp_')
    current_reference.add_ports(V_gn.ports, prefix = 'Vgn_')
    current_reference.add_ports(Tref.ports, prefix = 'Tref_')
    current_reference.add_ports(Pref.ports, prefix = 'Pref_')
    current_reference.add_ports(Nref.ports, prefix = 'Nref_')
    current_reference.add_ports(Tmoscap.ports, prefix = 'Tmoscap_')
    
    matrizn_currents_out = list()
    matrizp_currents_out = list()
    multipliers_total_n = len(matriz_n[0])
    multipliers_total_p = len(matriz_p[0])*2
    
    for multiplier in p_mirrors:
        result = []
        for row in matriz_p:
            new_row = row * multiplier  # repite la fila n veces
            result.append(new_row)
        matrizp_currents_out.append(result)
        print(result)
    for multiplier in n_mirrors:
        result = []
        for row in matriz_n:
            new_row = row * multiplier
            result.append(new_row)
        matrizn_currents_out.append(result)
        print(result)

    p_outs = list()
    n_outs = list()
    
    compensacion = list()
    
    if devices_info[0]['with_dummy']:
        multipliers_total_p += 4+2*len(p_mirrors)
        multipliers_total_n += 2+2*len(n_mirrors)
        row_compensacion_n = len(matriz_n)+2
        row_compensacion_p = len(matriz_p)+2
    else:
        row_compensacion_n = len(matriz_n)
        row_compensacion_p = len(matriz_p)
    
    for multiplier in p_mirrors:
        multipliers_total_p += len(matriz_p[0])*multiplier
    for multiplier in n_mirrors:
        multipliers_total_n += len(matriz_n[0])*multiplier
    
    print('Multiplicadores P:', multipliers_total_p)
    print('Multiplicadores N:', multipliers_total_n)
    
    if moscaps:
        if multipliers_total_p != multipliers_total_n:
            diferencia = multipliers_total_p - multipliers_total_n
            mag_diferencia =  abs(diferencia)
            exp = [1] * (mag_diferencia) 
            if diferencia > 0 and mag_diferencia != 0:
                if len(p_mirrors)>len(n_mirrors):
                    exp = [1] * (mag_diferencia+(len(p_mirrors)-len(n_mirrors)))
                for i in range(row_compensacion_n):
                    compensacion.append(exp)
                down = True
                up = False
                print('Se agregaran moscap N')
            elif diferencia < 0 and mag_diferencia != 0:
                if len(n_mirrors)>len(p_mirrors)+2:
                    exp = [1] * (mag_diferencia+((len(n_mirrors)-2)-len(p_mirrors)))  
                for i in range(row_compensacion_p):
                    compensacion.append(exp)
                down = False
                up = True
                print('Se agregaran moscap P')
            else:
                down = False
                up = False
                print('No se agregaran moscap')
        else:
            down = False
            up = False
            print('No se agregaran moscap')
    else:
        down = False
        up = False 
    
    placement_pouts = list()
    placement_nouts = list()
    Current_out_nums=0
    for matrix in matrizp_currents_out:
        #Transistor P
        p_outs.append(macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info[1]['type'], with_substrate_tap=devices_info[1]['with_substrate_tap'],
                                                              with_tie=devices_info[1]['with_tie'], width1=devices_info[1]['width'], length1=devices_info[1]['length'],
                                                              fingers1=devices_info[1]['fingers'], matriz=matrix, with_dummy=devices_info[1]['with_dummy'],
                                                              width_route_mult=devices_info[1]['width_route_mult'], with_lvt_layer=devices_info[1]['lvt'], full_output_size = True))
        placement_pouts.append(current_reference << p_outs[-1])
        #Calcular movex segun tamaño
        size_last_pout = evaluate_bbox(placement_pouts[-1])
        #Mover los componentes
        if len(placement_pouts) == 1:
            pmove_x += pdk.get_grule('met4')['min_separation'] + (size_Pref[0] + size_last_pout[0])/2
        else:
            size_pre_last_pout = evaluate_bbox(placement_pouts[-2])
            pmove_x += pdk.get_grule('met4')['min_separation'] + (size_pre_last_pout[0] + size_last_pout[0])/2
    
        if type_transistor_p==len(matriz_p[0]) or type_transistor_p==0:
            placement_pouts[-1].movey(-(pdk.snap_to_2xgrid(0.72)))
        placement_pouts[-1].movex(pmove_x)
        #guardar puertos
        current_reference.add_ports(placement_pouts[-1].get_ports_list(), prefix='pout_'+str(len(placement_pouts)))
        #Rutear drain-source
        ruta_ds_pouts = current_reference << L_route(pdk, placement_pouts[-1].ports['A_drain_E'], placement_pouts[-1].ports['B_source_N'])
        #Rutear bulk-VDD
        ruta_bvs = current_reference << straight_route(pdk, placement_pouts[-1].ports['bulk_down_N'], placement_pouts[-1].ports['A_source_S'])
        #Rutear gates
        if Current_out_nums==0:
            ruta_gates_pouts = current_reference << straight_route(pdk, Pref.ports['B_gate_W'], placement_pouts[-1].ports['A_gate_E'])
        else:
            pass
            ruta_gates_pouts = current_reference << straight_route(pdk, placement_pouts[-1].ports['A_gate_E'], placement_pouts[-2].ports['B_gate_W'])
        
        extensionPout = abs(placement_pouts[-1].ports['B_source_S'].center[1]-placement_pouts[-1].ports['A_gate_S'].center[1]) + pdk.get_grule('met2')['min_separation']
        ruta_gate_common = current_reference << c_route(pdk, placement_pouts[-1].ports['A_gate_S'], placement_pouts[-1].ports['B_gate_S'], extension=extensionPout, cglayer='met2') 
        Current_out_nums +=1
    Current_out_nums = 0
    print('Se realizo el placement de las salidas de corriente P')
    #Rutear sources
    ruta_sources_pouts = current_reference << straight_route(pdk, Pref.ports['A_source_W'], placement_pouts[-1].ports['A_source_E'])
    #rutear bulks
    ruta_bulks_pouts = current_reference << straight_route(pdk, Pref.ports['bulk_up_W'], placement_pouts[-1].ports['bulk_up_E'])

    #Quiero reflejar en x los espejos n para facilitar conectarlos
    for matrix in matrizn_currents_out:
        #Transistor N
        n_outs.append(macro_two_transistor_placement_Onchip(pdk=pdk, deviceA_and_B=devices_info[2]['type'], with_substrate_tap=devices_info[2]['with_substrate_tap'],
                                                              with_tie=devices_info[2]['with_tie'], width1=devices_info[2]['width'], length1=devices_info[2]['length'],
                                                              fingers1=devices_info[2]['fingers'], matriz=matrix, with_dummy=devices_info[2]['with_dummy'],
                                                              width_route_mult=devices_info[2]['width_route_mult'], with_lvt_layer=devices_info[2]['lvt'], full_output_size = True))
        placement_nouts.append(current_reference << n_outs[-1])
        #Calcular movex segun tamaño
        size_last_nout = evaluate_bbox(placement_nouts[-1])
        #Reflejar en x
        placement_nouts[-1].mirror((1,0))
        #Mover los componentes
        if len(placement_nouts) == 1:
            nmove_x += pdk.get_grule('met4')['min_separation'] + (size_Nref[0] + size_last_nout[0])/2
        else:
            size_pre_last_nout = evaluate_bbox(placement_nouts[-2])
            nmove_x += pdk.get_grule('met4')['min_separation'] + (size_pre_last_nout[0] + size_last_nout[0])/2
        placement_nouts[-1].movex(nmove_x)
        placement_nouts[-1].movey(-nmove_y)
        #guardar puertos
        current_reference.add_ports(placement_nouts[-1].get_ports_list(), prefix='nout_'+str(len(placement_nouts)))
        #Rutear drain-source
        ruta_ds_nouts = current_reference << L_route(pdk, placement_nouts[-1].ports['B_source_N'], placement_nouts[-1].ports['A_drain_W'])
        #Rutear bulk-VSS
        ruta_bvs = current_reference << straight_route(pdk, placement_nouts[-1].ports['bulk_down_N'], placement_nouts[-1].ports['A_source_S'])
        #Rutear gates
        if Current_out_nums==0:
            ruta_gates_nouts = current_reference << straight_route(pdk, Nref.ports['B_gate_W'], placement_nouts[-1].ports['A_gate_E'])
        else:
            pass
            ruta_gates_nouts = current_reference << straight_route(pdk, placement_nouts[-1].ports['A_gate_E'], placement_nouts[-2].ports['B_gate_W'])
        
        extensionNout = abs(placement_nouts[-1].ports['B_source_S'].center[1]-placement_nouts[-1].ports['A_gate_S'].center[1]) + pdk.get_grule('met2')['min_separation']
        ruta_gate_common = current_reference << c_route(pdk, placement_nouts[-1].ports['A_gate_S'], placement_nouts[-1].ports['B_gate_S'], extension=extensionNout, cglayer='met2') 

        Current_out_nums +=1
    Current_out_nums=0
    print('Se realizo el placement de las salidas de corriente N')
    #Rutear sources
    ruta_sources_nouts = current_reference << straight_route(pdk, Nref.ports['A_source_W'], placement_nouts[-1].ports['A_source_E'])
    #ruta bulks
    ruta_bulks_nouts = current_reference << straight_route(pdk, Nref.ports['bulk_up_W'], placement_nouts[-1].ports['bulk_up_E'])
    #Placement compensacion
    devices_info[1]['with_dummy'] = False
    devices_info[2]['with_dummy'] = False
    
    if up:
        compensacion_p = moscap(gf180, devices_info[1], compensacion)
        
        placement_compensacion = current_reference << compensacion_p
        size_compensacion_p = evaluate_bbox(compensacion_p)
        #Reflejar en y
        placement_compensacion.mirror((0,1))
        #Calcular movex segun tamaño
        pmove_x += pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + (size_last_pout[0] + size_compensacion_p[0])/2)
        #Mover los componentes
        placement_compensacion.movex(pmove_x)#.movey(pmove_y)
        print('Se realizo el placement de los moscap P')

    if down:
        compensacion_n = moscap(gf180, devices_info[2], compensacion)
        
        placement_compensacion = current_reference << compensacion_n
        size_compensacion_n = evaluate_bbox(compensacion_n)
        #Reflejar en x,y
        placement_compensacion.mirror((1,0))
        placement_compensacion.mirror((0,1))
        #Calcular movex segun tamaño
        nmove_x += pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + (size_last_nout[0] + size_compensacion_n[0])/2)
        #Mover los componentes
        if size_Tref[1]>= size_Pref[1]:
            nmove_y = pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + (size_Tref[1] + size_Nref[1])/2)
        else:
            nmove_y = pdk.snap_to_2xgrid(3*pdk.get_grule('met4')['min_separation'] + 2*evaluate_bbox(via_stack(pdk,'met2','met3'))[1] + (size_Pref[1] + size_Nref[1])/2)
        
        placement_compensacion.movex(nmove_x).movey(-nmove_y)
        #Ruteo VSS
        ruta_vssn = current_reference << L_route(pdk, placement_compensacion.ports['VS_S'], placement_nouts[-1].ports['A_source_W'])
        #Ruteo VDD
        ruta_vddn = current_reference << c_route(pdk, placement_compensacion.ports['VG_W'], placement_pouts[-1].ports['A_source_E'], cglayer='met1', extension=1.5)
        print('Se realizo el placement de los moscap N')
    
    current_reference_centered = center_component_with_ports(pdk, current_reference)
    component = Component()
    component << current_reference_centered

    boundary_dim = evaluate_bbox(component)
    #Temporal save port name
    rectangle_ref = rectangle((0.5,0.5), layer=pdk.get_glayer('met2'), centered=True)
    temp = Component()
    #Input port
    V_refp = current_reference_centered << rectangle_ref
    V_refp.movey(pdk.snap_to_2xgrid(current_reference_centered.ports['Tref_A_gate_W'].center[1]))
    V_refp.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    current_reference_centered << straight_route(pdk, current_reference_centered.ports['Tref_A_gate_E'], V_refp.ports['e1'])
    temp.add_ports(V_refp.get_ports_list(), prefix='V_refp_')
    temp = rename_ports_by_orientation(temp)
    current_reference_centered.add_ports(temp.get_ports_list())

    temp = Component()
    V_refn = current_reference_centered << rectangle_ref
    V_refn.movey(pdk.snap_to_2xgrid(current_reference_centered.ports['Vdp_bottom_met_W'].center[1]))
    V_refn.movex((pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    current_reference_centered << straight_route(pdk, current_reference_centered.ports['Vdp_bottom_met_W'], V_refn.ports['e3'])
    temp.add_ports(V_refn.get_ports_list(), prefix='V_refn_')
    temp = rename_ports_by_orientation(temp)
    current_reference_centered.add_ports(temp.get_ports_list())

    temp = Component()
    V_comn = current_reference_centered << rectangle_ref
    V_comn.movey(pdk.snap_to_2xgrid(current_reference_centered.ports['Tmoscap_VS_W'].center[1]))
    V_comn.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    current_reference_centered << straight_route(pdk, current_reference_centered.ports['Tmoscap_VS_E'], V_comn.ports['e1'])
    temp.add_ports(V_comn.get_ports_list(), prefix='V_comn_')
    temp = rename_ports_by_orientation(temp)
    current_reference_centered.add_ports(temp.get_ports_list())

    temp = Component()
    V_res = current_reference_centered << rectangle_ref
    V_res.movey(pdk.snap_to_2xgrid(current_reference_centered.ports['Tmoscap_VG_W'].center[1]))
    V_res.movex(-(pdk.snap_to_2xgrid(boundary_dim[0]/2-evaluate_bbox(rectangle_ref)[0]/2)))
    current_reference_centered << straight_route(pdk, current_reference_centered.ports['Tmoscap_VG_E'], V_comn.ports['e1'])
    temp.add_ports(V_res.get_ports_list(), prefix='V_res_')
    temp = rename_ports_by_orientation(temp)
    current_reference_centered.add_ports(temp.get_ports_list())

    route_list = [['Tref_A_source_T_Ver_R_','VDD'], ['Tref_A_source_T_Ver_L_','VDD'],['Pref_A_source_T_Ver_R_','VDD'], ['Pref_A_source_T_Ver_L_','VDD'],
                  ['Nref_A_source_T_Ver_R_','VSS'], ['Nref_A_source_T_Ver_L_','VSS']]
    
    for i in range(len(placement_pouts)):
        route = []
        route.append('pout_'+str(i+1)+'A_source_T_Ver_R_')
        route.append('VDD')
        route_list.append(route)
        route = []
        route.append('pout_'+str(i+1)+'A_source_T_Ver_L_')
        route.append('VDD')
        route_list.append(route)

    for i in range(len(placement_nouts)):
        route = []
        route.append('nout_'+str(i+1)+'A_source_T_Ver_R_')
        route.append('VSS')
        route_list.append(route)
        route = []
        route.append('nout_'+str(i+1)+'A_source_T_Ver_L_')
        route.append('VSS')
        route_list.append(route)
    
    
    for i in range(len(placement_pouts)):
        filtrar_puertos(current_reference_centered, component, 'pout_'+str(i+1)+'B_drain_', 'IREF'+str(i+1)+'p_')

    for i in range(len(placement_nouts)):
        filtrar_puertos(current_reference_centered, component, 'nout_'+str(i+1)+'B_drain_', 'IREF'+str(i+1)+'n_')
    
    filtrar_puertos(current_reference_centered, component, 'V_refp_', 'Opamp_output_')
    filtrar_puertos(current_reference_centered, component, 'V_refn_', 'VreferenceN_')
    filtrar_puertos(current_reference_centered, component, 'V_res_', 'Resistor_')
    filtrar_puertos(current_reference_centered, component, 'V_comn_', 'VCOMN_')

    for route in route_list:
        filtrar_puertos(current_reference_centered, component, route[0], signal=True)

    # add the pin and label
    for i in range(len(placement_pouts)):
        pin_label_creation(pdk, 'IREF'+str(i+1)+'p', 'Iref'+str(i+1)+'p', 'met3', component)
    for i in range(len(placement_nouts)):
        pin_label_creation(pdk, 'IREF'+str(i+1)+'n', 'Iref'+str(i+1)+'n', 'met3', component)
    pin_label_creation(pdk, 'VreferenceN', 'Vrefn', 'met2', component)
    pin_label_creation(pdk, 'Resistor', 'Vres', 'met3', component)
    
    return component, route_list

def generator_current_reference():
    # Information of the transistors

    m1 = {'type':'pfet', 'name':'M1', 'width':2, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':True}
    m2 = {'type':'pfet', 'name':'M2', 'width':2, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':True}
    m5 = {'type':'nfet', 'name':'M5', 'width':4, 'length':2, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':True, 'lvt':False}
    MC = {'type':'pfet', 'name':'MC', 'width':5, 'length':5, 'width_route_mult':1, 'fingers':1, 'with_substrate_tap':False, 'with_tie':True, 'with_dummy':False, 'lvt':False}
    devices_info = [m1, m2, m5, MC]
    matriz1 = [[1,2],[2,1]]
    matriz2_p = [[1,2],[2,1]]
    #Por conveniencia de diseño matriz1=matriz2_p para mejorar la distribución de layout
    matriz3_n = [[1,2],[2,1]]
    pmirror = [1,10,25]
    nmirror = [1,10,25]
    MC_array = [[1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1],[1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1,1]]    

    current_outs, rails_route_list = current_reference(gf180, devices_info, matriz1, matriz2_p, matriz3_n, pmirror, nmirror, MC_array, moscaps=True)
    # Display the current mirror layout at Klayout:
    #current_reference.name = "current_reference"
    #current_reference.write_gds("current_reference_pcells.gds")
    #current_outs.show()
    # display_component(current_outs, "current_reference_pcells")
    return current_outs, rails_route_list

#if __name__ == "__main__":
    # If called directly call main function
    # generator_current_reference()


# Final Circuit Layout

This code builds and exports the complete layout of a CMOS operational transconductance amplifier (OTA), integrating its biasing circuit and current reference into a single physical block.

The OTA_Current_Reference function instantiates three previously generated subcircuits (generator_bias, generator_core, and generator_current_reference), places them in the layout in accordance with the PDK design rules, and adjusts their positions to properly align the biasing ports and avoid routing conflicts. It then performs all internal routing between these blocks.

Subsequently, the entire circuit is centered, surrounded by the corresponding technological boundary layer, and equipped with horizontal and vertical power rails (VDD and VSS) through the power_rails_placement function, which connects all internal branches specified in the routing lists. Finally, the ports are filtered and renamed to expose a clean set of top-level terminals (VREF, VBIASP1, VBIASP2, VBIASN1, VBIASN2, differential inputs P_V+ and P_V−, output P_Vout, common-mode node, VDD, and VSS), and pin geometries and labels are created in the corresponding metal layers.

In the final section, the code calls OTA_Current_Reference using the GF180 PDK, assigns a name to the resulting component, generates the complete GDSII layout file (current_reference_generator_v2_pcells.gds), and graphically displays the result

In [11]:
def OTA_Current_Reference(pdk: MappedPDK,
                        width_route: float = 0) -> Component:
    """
    this function connects the biasing and core circuits of the OTA to current reference circuit
    """
    # Create the component
    OTA_Current_Reference = Component()
    Bias_circuit, bias_route_list = generator_bias()
    Core_circuit, core_route_list = generator_core()
    current_reference, current_route_list = generator_current_reference()
    Bias = OTA_Current_Reference << Bias_circuit
    Core = OTA_Current_Reference << Core_circuit
    Current_Outputs = OTA_Current_Reference << current_reference

    Bias_size =  evaluate_bbox(Bias)
    Core_size =  evaluate_bbox(Core)
    Current_Outputs_size = evaluate_bbox(Current_Outputs)

    min_separation_nwell = pdk.get_grule('nwell')['min_separation']
    min_separation2 = pdk.get_grule('met2')['min_separation']
    min_separation3 = pdk.get_grule('met3')['min_separation']

    #Movement and Aux vias
    via_23 = via_stack(pdk, 'met2', 'met3')
    size_via23 = evaluate_bbox(via_23)

    Core_HMovement = (Bias_size[0] + Core_size[0])/2 + 2*size_via23[0] + 4*min_separation3
    Core_VMovement = (Core_size[1]/2)-(Bias_size[1]/2)
    Current_HMovement = ((Bias_size[0]/2) + Core_size[0] + (Current_Outputs_size[0]/2) + 4*size_via23[0] + 8*min_separation3)
    Current_VMovement = (Current_Outputs_size[1]/2)-(Bias_size[1]/2)

    Core.movex(pdk.snap_to_2xgrid(Core_HMovement))
    Core.movey(pdk.snap_to_2xgrid(Core_VMovement))
    Current_Outputs.movex(pdk.snap_to_2xgrid(Current_HMovement))
    Current_Outputs.movey(pdk.snap_to_2xgrid(Current_VMovement))
    
    #algin movement
    port_biasv1n_core = Core.ports["P_VbiasN1_E"].center[1]
    port_biasv1n_bias = Bias.ports["VBIASN1_E"].center[1]
    port_biasv2n_bias = Bias.ports["VBIASN2_E"].center[1]
    port_biasv1p_bias = Bias.ports["VBIASP1_E"].center[1]
    port_biasv2p_bias = Bias.ports["VBIASP2_E"].center[1]

    extra_move = 0
    unavailable_pos = [port_biasv1n_core-0.25-min_separation2-width_route/2, port_biasv1n_core+0.25+min_separation2+width_route/2]

    ports_check = [port_biasv1n_bias, port_biasv2n_bias, port_biasv1p_bias, port_biasv2p_bias]
    for port in ports_check:
        if unavailable_pos[0] < port < unavailable_pos[1]:
            extra_move -= round(width_route + 1 + 2*min_separation2, 2) 
            print(f'extra move {extra_move}')
            Core.movey(pdk.snap_to_2xgrid(extra_move))

    Core.movex(0.0001)
    Core.movey(0.0001)

    Bias.movex(0.001)
    Bias.movey(0.001)  

    aux_N1 = OTA_Current_Reference << via_23
    aux_N1.movey(Bias.ports['VBIASN1_E'].center[1])
    aux_N1.movex(Bias.ports['VBIASN1_N'].center[0])

    aux_P2 = OTA_Current_Reference << via_23
    aux_P2.movey(Bias.ports['VBIASP2_E'].center[1])
    aux_P2.movex(Bias.ports['VBIASP2_N'].center[0] + size_via23[0] + min_separation3)
    OTA_Current_Reference << straight_route(pdk, Bias.ports['VBIASP2_E'], aux_P2.ports['bottom_met_W'])

    aux_N2 = OTA_Current_Reference << via_23
    aux_N2.movey(Bias.ports['VBIASN2_E'].center[1])
    aux_N2.movex(Bias.ports['VBIASN2_N'].center[0] + 2*size_via23[0] + 3*min_separation3)
    OTA_Current_Reference << straight_route(pdk, Bias.ports['VBIASN2_E'], aux_N2.ports['bottom_met_W'])

    aux_Vref = OTA_Current_Reference << via_23
    aux_Vref.movey(Bias.ports['VREF_E'].center[1])
    aux_Vref.movex(Bias.ports['VREF_N'].center[0])

    aux_Vcom = OTA_Current_Reference << via_23
    aux_Vcom.movey(Current_Outputs.ports['VCOMN_E'].center[1])
    aux_Vcom.movex(Current_Outputs.ports['VCOMN_N'].center[0] - size_via23[0] - min_separation3)
    OTA_Current_Reference << straight_route(pdk, Current_Outputs.ports['VCOMN_E'], aux_Vcom.ports['bottom_met_W'])

    aux_Vrep = OTA_Current_Reference << via_23
    #aux_Vrep.movey(Current_Outputs.ports['Opamp_output_E'].center[1])
    aux_Vrep.movey(Current_Outputs.ports['VCOMN_E'].center[1])
    aux_Vrep.movex(Current_Outputs.ports['Opamp_output_N'].center[0] - size_via23[0] - min_separation2)
    aux_Vrep.movey(-(pdk.snap_to_2xgrid(size_via23[1])))
    aux_Vrep.movex(-(pdk.snap_to_2xgrid(size_via23[0]+pdk.get_grule('met3')['min_separation'])))
    OTA_Current_Reference << L_route(pdk, Current_Outputs.ports['Opamp_output_E'], aux_Vrep.ports['bottom_met_S'], vglayer='met3')

    aux_Vres = OTA_Current_Reference << via_23
    #aux_Vres.movey(Current_Outputs.ports['Resistor_E'].center[1])
    aux_Vres.movey(Current_Outputs.ports['VCOMN_E'].center[1])
    aux_Vres.movex(Current_Outputs.ports['Resistor_N'].center[0])
    aux_Vres.movey(-(pdk.snap_to_2xgrid(2*size_via23[1]+pdk.get_grule('met3')['min_separation'])))
    OTA_Current_Reference << straight_route(pdk, Current_Outputs.ports['Resistor_N'], aux_Vres.ports['bottom_met_S'], glayer1='met3')

    OTA_Current_Reference.add_ports(Bias.get_ports_list(),prefix='Bias_')
    OTA_Current_Reference.add_ports(Core.get_ports_list(),prefix='Core_')
    OTA_Current_Reference.add_ports(Current_Outputs.get_ports_list(),prefix='Current_Outs_')
    port = [name for name in Current_Outputs.ports if 'Nref_A_source_T_Ver' in name]
    print (port)
    #Routing

    OTA_Current_Reference << L_route(pdk, aux_N1.ports['top_met_S'], Core.ports['P_VbiasN1_E'])
    OTA_Current_Reference << L_route(pdk, aux_N2.ports['top_met_N'], Core.ports['P_VbiasN2_E'])
    OTA_Current_Reference << L_route(pdk, aux_P2.ports['top_met_N'], Core.ports['P_VbiasP2_E'])
    OTA_Current_Reference << L_route(pdk, Core.ports['P_Vcomn_W'], aux_Vcom.ports['top_met_S'], vglayer='met3')
    OTA_Current_Reference << L_route(pdk, Core.ports['P_Vout_W'], aux_Vrep.ports['top_met_S'], vglayer='met3')
    OTA_Current_Reference << L_route(pdk, Core.ports['P_V-_E'], Bias.ports['VREF_S'], vglayer='met3')
    OTA_Current_Reference << L_route(pdk, Core.ports['P_V+_N'], aux_Vres.ports['top_met_E'], hglayer='met2')
    
    OTA_centered = center_component_with_ports(pdk, OTA_Current_Reference)
    boundary = Boundary_layer(pdk, OTA_centered)
    
    #Rails
    route_list_hor = list()
    route_list_ver = list()
    #bias
    for route in bias_route_list:
        new_name = 'Bias_' + route[0]
        route[0] = new_name
        route_list_hor.append(route)

    #core
    for route in core_route_list:
        new_name =  'Core_' + route[0]
        route[0] = new_name
        route_list_hor.append(route)

    #current
    for route in current_route_list:
        new_name =  'Current_Outs_' + route[0]
        route[0] = new_name
        route_list_hor.append(route)
    
    port = [name for name in OTA_centered.ports if 'Nref_A_source_T_Ver' in name]
    print (port)
    power_rails_placement(pdk = pdk,
                          component = OTA_centered,
                          width = 1.2,
                          alignment = 0,    #0 horizontal
                          route_list = route_list_hor,
    #                      specific_rail=specific_rail,
                          label = False,
                          ports = True)
    
    ports_VDD = [name for name in OTA_centered.ports if 'VDD' in name and 'W' in name]
    ports_VSS = [name for name in OTA_centered.ports if 'VSS' in name and 'W' in name]

    for i in range(len(ports_VDD)):
        route = []
        route.append(ports_VDD[i][0:-1])
        route.append('VDD')
        route_list_ver.append(route)
    
    for i in range(len(ports_VSS)):
        route = []
        route.append(ports_VSS[i][0:-1])
        route.append('VSS')
        route_list_ver.append(route)
    
    power_rails_placement(pdk = pdk,
                          component = OTA_centered,
                          width = 1.2,
                          alignment = 1,    #1 vertical
                          route_list = route_list_ver,
                          label = False,
                          ports = False)

    component = Component()
    component << OTA_centered

    #Ports and label biasing
    filtrar_puertos(OTA_centered, component, 'Bias_VREF_', 'VREF_', True)
    filtrar_puertos(OTA_centered, component, 'Bias_VBIASN1_', 'VBIASN1_', True)
    filtrar_puertos(OTA_centered, component, 'Bias_VBIASN2_', 'VBIASN2_', True)
    filtrar_puertos(OTA_centered, component, 'Bias_VBIASP1_', 'VBIASP1_', True)
    filtrar_puertos(OTA_centered, component, 'Bias_VBIASP2_', 'VBIASP2_', True)
   
    pin_label_creation(pdk, 'VREF', 'Vref', 'met2', component)    

    #Ports and label core
    filtrar_puertos(OTA_centered, component, 'Core_P_V+_', 'P_V+_', True)
    filtrar_puertos(OTA_centered, component, 'Core_P_V-_', 'P_V-_', True)
    filtrar_puertos(OTA_centered, component, 'Core_P_VbiasN1_', 'P_VbiasN1_', True) 
    filtrar_puertos(OTA_centered, component, 'Core_P_Vout_', 'P_Vout_', True)
    filtrar_puertos(OTA_centered, component, 'Core_P_VbiasP2_', 'P_VbiasP2_', True) 
    filtrar_puertos(OTA_centered, component, 'Core_P_VbiasN2_', 'P_VbiasN2_', True)  
    filtrar_puertos(OTA_centered, component, 'Core_P_Vcomn_', 'P_Vcomn_', True)

    pin_label_creation(pdk, 'P_Vout','Vrefp','met2',component)


    #VDD and VSS
    filtrar_puertos(OTA_centered, component, 'VDD_2_', 'VDD_P_')
    filtrar_puertos(OTA_centered, component, 'VSS_1_', 'VSS_P_')
    pin_label_creation(pdk, 'VDD_P', 'VDD', 'met4', component)
    pin_label_creation(pdk, 'VSS_P', 'VSS', 'met4', component)
    
    return component_snap_to_grid(component)


Test = OTA_Current_Reference(gf180, 1)
Test.name = "current_reference_generator_v2"
Test.write_gds("current_reference_generator_v2_pcells.gds")
display_component(Test, "out")
#Test.show()

2025-11-05 03:59:34.102 | WARNING  | gdsfactory.pdk:get_active_pdk:733 - No active PDK. Activating generic PDK.



dummys M1 = 10
dummys M2 = 10
dummys M3 = 12
dummys M4 = 10
dummys M5 = 10
dummys M6 = 12
dummys M7 = 104


2025-11-05 03:59:34.583 | INFO     | gdsfactory.technology.layer_views:__init__:790 - Importing LayerViews from YAML file: '/headless/conda-env/miniconda3/envs/GLdev/lib/python3.10/site-packages/gdsfactory/generic_tech/layer_views.yaml'.
2025-11-05 03:59:34.585 | INFO     | gdsfactory.pdk:activate:337 - 'generic' PDK is now active
2025-11-05 03:59:34.597 | INFO     | gdsfactory.pdk:activate:337 - 'gf180' PDK is now active


0
Port VREF_ filtered and added to the component.
Port VBIASN1_ filtered and added to the component.
Port VBIASN2_ filtered and added to the component.
Port VBIASP1_ filtered and added to the component.
Port VBIASP2_ filtered and added to the component.
bi_cur_dum_up = 12
bi_cur_dum_down = 12
Casc dum up = 10
Casc dum down = 12
Par = 50
Bias = 46
(29.78, 64.12)
(26.78, 54.16)
Port P_V+_ filtered and added to the component.
Port P_V-_ filtered and added to the component.
Port P_VbiasN1_ filtered and added to the component.
Port P_Vout_ filtered and added to the component.
Port P_VbiasP2_ filtered and added to the component.
Port P_VbiasN2_ filtered and added to the component.
Port P_Vcomn_ filtered and added to the component.
Transistores de referencia creados
[[1, 2], [2, 1]]
[[1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2], [2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1]]
[[1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1, 2, 1,

2025-11-05 04:07:45.918 | INFO     | gdsfactory.component:_write_library:1851 - Wrote to 'current_reference_generator_v2_pcells.gds'
